# INSTRUCTIONS

* Run all cells in **Definitions**, **Particles**, and **Reactions**
  
  --> Inspect what you got.

* In case of no image or an error, re-run that cell to redisplay.



# **Definitions**:

In [2]:
#@title AUXILLARY FUNCTIONS
import numpy as np
from scipy.spatial.transform import Rotation as R

# Constants
meson_number_of_coils = 139  # to include space for gluons at one end

#plot points per quanta
plot_resolution = 20

def get_normal_vector(p1, p2, p3):
    """
    Calculate the normal vector of a surface defined by three points.

    Parameters:
    ----------
    p1, p2, p3 : array-like
        Three points on the surface, each specified as an iterable (e.g., list, tuple, or numpy array) of x, y, z coordinates.

    Returns:
    -------
    normal_vector : numpy.ndarray
        A 3D vector representing the normal to the surface. The vector is not normalized.

    """
    # Convert points to numpy arrays
    p1, p2, p3 = np.array(p1), np.array(p2), np.array(p3)

    # Define two vectors on the surface
    v1 = p2 - p1
    v2 = p3 - p1

    # Calculate the cross product to find the normal vector
    normal_vector = np.cross(v1, v2)

    return normal_vector

def angle_between_vectors(u, v):
    """
    Calculate the angle between two vectors using the cross product.

    Parameters:
    u, v : array-like
        Input vectors.

    Returns:
    tuple
        The angle between the vectors in radians and degrees.
    """
    u = np.array(u)
    v = np.array(v)

    cross_product = np.cross(u, v)
    magnitude_u = np.linalg.norm(u)
    magnitude_v = np.linalg.norm(v)
    magnitude_cross = np.linalg.norm(cross_product)

    sin_theta = magnitude_cross / (magnitude_u * magnitude_v)
    sin_theta = np.clip(sin_theta, -1.0, 1.0)  # Ensure sin_theta is within the valid range

    angle_radians = np.arcsin(sin_theta)

    return angle_radians

def to_local(point_global, origin_global, x_local, y_local, z_local, scale_local=np.array([1, 1, 1])):
    """Transforms a point from the global coordinate system to the local coordinate system.

    Args:
        point_global: A numpy array representing the point in the global coordinate system.
        origin_global: A numpy array representing the origin of the local coordinate system in the global coordinate system.
        x_local: A numpy array representing the x-axis unit vector of the local coordinate system in the global coordinate system.
        y_local: A numpy array representing the y-axis unit vector of the local coordinate system in the global coordinate system.
        z_local: A numpy array representing the z-axis unit vector of the local coordinate system in the global coordinate system.
        scale_local: A numpy array representing the scaling factors for the x, y, and z axes of the local coordinate system.

    Returns:
        A numpy array representing the point in the local coordinate system.
    """
    # Create the transformation matrix
    rotation_matrix = np.array([x_local, y_local, z_local]).T
    translation_vector = -np.dot(rotation_matrix, origin_global)
    transformation_matrix = np.vstack(
        [np.hstack([rotation_matrix, translation_vector.reshape(3, 1)]), [0, 0, 0, 1]])

    # Transform the point
    point_global_homogeneous = np.append(point_global, 1)
    point_local_homogeneous = np.dot(transformation_matrix, point_global_homogeneous)
    point_local = point_local_homogeneous[:3] / scale_local

    return point_local


def to_global(point_local, origin_global, x_local, y_local, z_local, scale_local=np.array([1, 1, 1])):
    """Transforms a point from the local coordinate system to the global coordinate system.

    Args:
        point_local: A numpy array representing the point in the local coordinate system.
        origin_global: A numpy array representing the origin of the local coordinate system in the global coordinate system.
        x_local: A numpy array representing the x-axis unit vector of the local coordinate system in the global coordinate system.
        y_local: A numpy array representing the y-axis unit vector of the local coordinate system in the global coordinate system.
        z_local: A numpy array representing the z-axis unit vector of the local coordinate system in the global coordinate system.
        scale_local: A numpy array representing the scaling factors for the x, y, and z axes of the local coordinate system.

    Returns:
        A numpy array representing the point in the global coordinate system.
    """

    # Create the inverse transformation matrix
    rotation_matrix = np.array([x_local, y_local, z_local]).T
    translation_vector = origin_global
    transformation_matrix = np.vstack(
        [np.hstack([rotation_matrix, translation_vector.reshape(3, 1)]), [0, 0, 0, 1]])

    # Scale the point
    point_local = point_local * scale_local

    # Transform the point
    point_local_homogeneous = np.append(point_local, 1)
    point_global_homogeneous = np.dot(transformation_matrix, point_local_homogeneous)
    point_global = point_global_homogeneous[:3]

    return point_global


def particle_arc(arc_length, total_length, major_radius, minor_radius, coil_handedness, major_start,annihilation_pitch):
    """
    Generate an arc based on particle properties
    """
    if arc_length==0:
        return np.array([])
    #Keep same resolution as with minor windings
    num_points = int(plot_resolution*3/2)
    arc_length = arc_length*coil_handedness
    major_stop= arc_length / total_length * 2 * np.pi+major_start

    theta = np.linspace(start=major_start, stop=major_stop, num=num_points)  # Major circle parameter

    x = np.cos(theta)*major_radius
    y = np.sin(theta)*major_radius
    z = np.zeros(num_points)


    #Adjust theta so that the end of the coil stays in fixed position when annihilating.
    theta -= major_stop

    # Annihilation pitch for the whole torus.
    z -= annihilation_pitch * theta/np.pi

    return np.stack([x,y,z],axis=1)


def get_num_helix_points(num_quanta):
    """
    Return number of points for helix so that each quanta has plot_resolution points
    """
    return int(plot_resolution*num_quanta+1) #+1 is for num_quanta edges in curve

def helix_along_circle(arc_windings, total_windings, major_radius, minor_radius, coil_handedness,major_start,minor_start=0,num_quanta=0,amplitude=0,period=0,annihilation_pitch=0):
    """
    Generate the 3D coordinates of a torus with specified windings.
    """
    #Number plot resolution is number of points per winding
    num_points = get_num_helix_points(num_quanta)
    arc_windings=arc_windings*coil_handedness
    major_stop=arc_windings / total_windings * 2 * np.pi+major_start
    minor_stop=arc_windings * 2 * np.pi+minor_start

    theta = np.linspace(start=major_start, stop=major_stop, num=num_points)  # Major circle parameter
    phi =   np.linspace(start=minor_start, stop=minor_stop, num=num_points)  # Minor circle parameter (helical windings)
    """
    # Parametric equations for a torus
    x = (major_radius + minor_radius * np.cos(phi)) * np.cos(theta)
    y = (major_radius + minor_radius * np.cos(phi)) * np.sin(theta)
    if arc_windings > 0:
        z = minor_radius * np.sin(phi)  # Right-handed torus
    else:
        z = -minor_radius * np.sin(phi)  # Left-handed torusz = minor_radius * np.sin(phi)
    """
    # Parametric equations for a torus.
    # Annihilation pitch for the whole torus.
    x = (major_radius + minor_radius * np.cos(phi)) * (np.cos(theta)+amplitude*minor_radius * np.cos(period*phi))
    y = (major_radius + minor_radius * np.cos(phi)) * (np.sin(theta)+amplitude*minor_radius * np.cos(period*phi))


    #Adjust theta so that the end of the coil stays in fixed position when annihilating.
    theta -= major_stop

    if arc_windings > 0:
        z = minor_radius * np.sin(phi) -annihilation_pitch * theta/np.pi # Right-handed torus
    else:
        z = -minor_radius * np.sin(phi) -annihilation_pitch * theta/np.pi # Left-handed torus

    return np.stack([x,y,z],axis=1)


def fit_curve_to_position(position, curve):
    n1 = (position.rotationVector)/np.linalg.norm(position.rotationVector)
    n2 = (position.normalVector)/np.linalg.norm(position.normalVector)

    z_uv = -n2
    y_uv = np.cross(n1,n2)
    x_uv = n1

    curve = np.array([to_global(p, position.origin, x_uv,y_uv, z_uv) for p in curve])
    return curve

def fit_helix_to_triangle(triangle, helix):
    """
    Fit the Helix particle inside a given triangle
    """
    a = triangle[0]
    b = triangle[1]
    c = triangle[2]

    center = (a + b + c) / 3

    # Unit vectors for local coordinate system
    n1 = (b-a)/np.linalg.norm(b-a)
    n2 = (c-center)/np.linalg.norm(c-center)

    z_uv = np.cross(n1, n2)
    y_uv = np.cross(z_uv, n1)
    x_uv = n1

    # Trasnform to global system
    helix = np.array([to_global(p, center, x_uv,y_uv, z_uv) for p in helix])

    return helix

def calculate_helix_pitch(arc_windings, total_windings, major_radius, minor_radius):
    """
    Calculate the pitch (distance between adjacent coils along the outer edge of the helix).

    Parameters:
        arc_windings (float): Number of minor windings per major winding.
        total_windings (float): Total number of major windings around the torus.
        major_radius (float): Radius of the major circle of the torus.
        minor_radius (float): Radius of the minor circle of the torus.

    Returns:
        float: The pitch (distance between adjacent coils along the outer edge of the helix).
    """
    # Outer radius of the torus
    outer_radius = major_radius + minor_radius

    # Pitch formula
    pitch = (outer_radius) * (arc_windings / total_windings) * 2 * np.pi

    return pitch

def intersect_2d_arrays(*arrays):
    """
    Returns the intersection of multiple 2D numpy arrays (common rows).

    Parameters:
        *arrays: Variable number of 2D numpy arrays.

    Returns:
        np.ndarray: A 2D numpy array containing rows present in all arrays.
    """
    if len(arrays) < 2:
        raise ValueError("At least two arrays must be provided.")

    # Check if all inputs are 2D arrays
    for arr in arrays:
        if arr.ndim != 2:
            raise ValueError("All input arrays must be 2D.")

    # Use view as structured array for row-wise comparison
    dtype = np.dtype((np.void, arrays[0].dtype.itemsize * arrays[0].shape[1]))

    # Convert all arrays to structured views
    views = [np.ascontiguousarray(arr).view(dtype) for arr in arrays]

    # Find intersection iteratively
    common_rows_view = views[0]
    for view in views[1:]:
        common_rows_view = np.intersect1d(common_rows_view, view)

    # Convert back to original 2D array form
    if common_rows_view.size == 0:
        return np.empty((0, arrays[0].shape[1]), dtype=arrays[0].dtype)

    common_rows = common_rows_view.view(arrays[0].dtype).reshape(-1, arrays[0].shape[1])

    return common_rows

def flatten_with_nan_delimiter(list_3d):
    result = []
    for sublist in list_3d:
        for item in sublist:
            result.append(item)  # Add each 2D sublist
        result.append([np.nan] * len(result[0]))  # Add delimiter row of NaNs
    result.pop()  # Remove the last delimiter
    return result

def pop_rows_by_value(array, rows_to_remove):
    """
    Remove rows from a 2D NumPy array that match any of the given rows by value.

    Parameters:
    array (numpy.ndarray): The original 2D array.
    rows_to_remove (list or numpy.ndarray): List of rows to remove, each row as a list or 1D array.

    Returns:
    numpy.ndarray: A new array with the specified rows removed.
    """
    # Convert rows_to_remove to a NumPy array for easy comparison
    rows_to_remove = np.array(rows_to_remove)

    # Create a mask for rows to keep
    mask = np.ones(len(array), dtype=bool)
    for row in rows_to_remove:
        # Find indices of rows that match the current row
        matching_indices = np.where((array == row).all(axis=1))[0]
        mask[matching_indices] = False  # Mark these rows to be removed

    # Return the array with rows removed
    return array[mask]


In [3]:
#@title PARTICLE POSITIONING
class ParticlePosition():
    """
    A class that represents the position and orientation of a particle in 3D space.

    Attributes:
        anchor (int): Defines what part of torus should be pointed towards rotation vector. Possible values are anchor_opening (center of torus opening), anchor_start and anchor_end (start and end of helix)
        origin (numpy.ndarray): The 3D coordinates of the particle's origin. Default is `[0, 0, 0]`.
        rotationVector (numpy.ndarray): The 3D vector defining the particle's rotation along major axis. The point along torus defined by anchor is pointed towards rotation vector Default is `[1, 0, 0]`.
          for example if anchor is anchor_end, then rotationVector is vector from center to end of helix
        normalVector (numpy.ndarray): The 3D vector representing torus plane normal. Default is `[0, 0, 1]`. This should be replaced with just +/- sign as it's redundant to compute vectors after rotation vector is known.
        minorOrientation (float): Torus minor orientation angle. Default is `0`.
        anchor gluon (int) 0 or 1. Tells if gluon half should be considered when aligning anchor position to rotation vector.
    """
    anchor_opening=0
    anchor_start=1
    anchor_end=-1


    def __init__(self,anchor=anchor_opening,origin=np.array([0,0,0]),rotationVector=np.array([1,0,0]),normalVector=np.array([0,0,1]),minorOrientation=0,anchor_gluon=0):

        self.anchor=anchor
        self.origin=origin.astype(float)
        self.rotationVector=rotationVector/np.linalg.norm(rotationVector).astype(float)
        self.normalVector=normalVector/np.linalg.norm(normalVector).astype(float)
        self.minorOrientation=float(minorOrientation)
        self.anchor_gluon = anchor_gluon


In [4]:
#@title ELEMENTARY PARTICLE CLASSES

class ElementaryParticle:
    quanta:int=0
    position:ParticlePosition=False
    coilHandedness:int=0
    spinRadius:int = 1
    right_handedness = -1
    left_handedness = 1

    def isQuark(self):
        return self.coilHandedness==ElementaryParticle.left_handedness

    def setParticlePosition(self,position:ParticlePosition):
        self.position=position

    def get_quanta_indices(quanta:int):
        """
        Returns indeces at which quanta changes to next along helix curve returned by getHelix()
        """
        num_helix_points =get_num_helix_points(quanta)
        if quanta==1:
            return np.array([-1])
        else:
            return np.linspace(num_helix_points/quanta,num_helix_points-1,quanta,dtype=int)

    def getQuantaIndices(self):
        return HelixParticle.get_quanta_indices(self.quanta)

    def __init__(self):
        self.setParticlePosition(ParticlePosition())


class Gen1():
    amplitude:float = 0
    period:float = 0
    coilGeneration:int = 1

class Gen2():
    amplitude:float = 0.02
    period:float = 2
    coilGeneration:int = 2

class Gen3():
    amplitude:float = 0.02
    period:float = 4
    coilGeneration:int = 3


class HelixParticle(Gen1,ElementaryParticle):
    """
    Abstract class for single coil helix along torus particle from which electron, up, down etc. particles are inherited
    """

    helixRadius:float = ElementaryParticle.spinRadius
    torusRadius:float = np.pi
    windings:int = 0 #By setting windings and total windings to 0 we make sure that they have to be properly defined when inheriting class
    totalWindings:int=0
    majorOrientation=0
    amplitude=0
    period=0

    def __init__(self):
        #initialize middle of coil opening towards +x
        super().__init__()
        self.annihilationPitch=0

        self._updateMajorOrientation()

    def setTotalWindings(self, totalWindings):
        self.totalWindings=totalWindings
        self._updateMajorOrientation()

    def _updateMajorOrientation(self):
        self.majorOrientation=np.pi*(1-(self.windings*self.coilHandedness)/self.totalWindings)


    def isQuark(self):
        """
        Returns True if quark, False if antiquark
        """

        if self.windings == OpenTorus.totalWindings//3 and self.coilHandedness==ElementaryParticle.left_handedness or \
        self.windings==2*OpenTorus.totalWindings//3 and self.coilHandedness==ElementaryParticle.right_handedness:
            return True
        return False

    def positionFromTrianglePlane(self,triangle_plane):

        center = np.sum(triangle_plane,axis=0)/3
        opening_v = (triangle_plane[0]-center)*-self.coilHandedness
        edge2 = triangle_plane[1]-triangle_plane[2]
        normal_vector = -self.coilHandedness*np.cross(edge2,opening_v)
        normal_vector = normal_vector/np.linalg.norm(normal_vector)

        return ParticlePosition(origin=center,rotationVector=opening_v,normalVector=normal_vector)


    def getCurveLength(self):
        """
        Return length along curve.
        """
        helix=self.getHelix()
        distances=[np.linalg.norm(helix[i+1]-helix[i]) for i in range(len(helix)-1)]
        return np.sum(distances)


    def getMajorOrientation(self):
        """
        Returns torus major axis angle in radians. Adjusted depending if coil start, end or center of opening should align with rotation vector defined by particle position
        """
        mo = self.majorOrientation
        if self.position:
            if not self.position.anchor_gluon:
                #If we don't consider gluons we want to rotate by half of the coil length of the particle
                mo+=self.coilHandedness*self.position.anchor* 2*np.pi*(self.windings/self.totalWindings)/2
            else:
                #If we want to align gluons, we simply say that our particle + gluon halves should take in total 1/3 or 2/3rds of circle -> we rotate by 1/6th or 1/3rds from opening anchor.
                mo+=self.coilHandedness*self.position.anchor*np.pi*round((self.windings/self.totalWindings) * 3) / 3

        #Normalize orientation between -pi and pi
        return mo

    def getMinorOrientation(self):
        try:
            return self.position.minorOrientation
        except:
            return 0

    def getMinorAxisArc(self):
        """
        Returns the arc along the minor axis of torus
        """
        arc = particle_arc(self.windings,self.totalWindings,self.torusRadius,self.helixRadius,self.coilHandedness,self.getMajorOrientation(),self.annihilationPitch)
        if self.position:
            arc = fit_curve_to_position(self.position, arc)
        return arc

    def getTorusCenter(self):
        center = np.array([0,0,0])
        if self.position:
            center = fit_curve_to_position(self.position,[center])[0]
        return center

    def getNormalVector(self):
        """
        Returns normal vector.
        The normal multiplied by curve length and by handedness give the magnitude and sign of a magnetic moment,
        which sum up the total magnetic moment of a complex string.

        Loop normals' pairwise minimum sum is proportional to the mass of a string without abrupt changes.
        """
        #normal_vector = np.array([0,0,self.coilHandedness*np.pi])
        if self.position:
            return self.position.origin+self.position.normalVector
        return np.array([])


    def getHelix(self):
        """
        Return [[x1,y2,y3],[x2,y2,y3]] points for a curved helix inside a triangle

        """
        # Get helix in local coordinates with torus center being in (0,0,0)
        helix_points = helix_along_circle(
            arc_windings=self.windings,
            total_windings=self.totalWindings,
            major_radius=self.torusRadius,
            minor_radius=self.helixRadius,
            coil_handedness=self.coilHandedness,
            major_start=self.getMajorOrientation(),
            minor_start=self.getMinorOrientation(),
            num_quanta=self.quanta,
            annihilation_pitch=self.annihilationPitch,
            amplitude=self.amplitude,
            period=self.period,

            )

        if self.position:
            helix_points = fit_curve_to_position(self.position, helix_points)

        return helix_points

class OpenTorus(HelixParticle):
    totalWindings=138
    windings = 137
    quanta = 138

class ClosedTorus(HelixParticle):
    totalWindings=137
    windings = 137
    quanta = 138

class OneThirdTorus(ClosedTorus):
    quanta=OpenTorus.quanta//3
    windings=OpenTorus.totalWindings//3

class TwoThirdsTorus(ClosedTorus):
    quanta=OpenTorus.quanta*2//3
    windings=OpenTorus.totalWindings*2//3

class Photon(ElementaryParticle):
    coilHandedness = ElementaryParticle.left_handedness
    quanta=1
    windings=1
    totalWindings=1
    name = "Photon"

    def getHelix(self):
        """
        Photon isn't a helix...
        """
        r = ElementaryParticle.spinRadius
        t = np.linspace(-np.pi, np.pi, get_num_helix_points(self.quanta))

        wave1 = np.stack([t, np.zeros_like(t), self.coilHandedness * r * np.sin(t)], axis=1)
        wave2 = np.stack([t, self.coilHandedness * r * np.sin(t), np.zeros_like(t)], axis=1)

        return np.append(wave1,wave2,axis=0)

class AntiPhoton(Photon):
    coilHandedness = ElementaryParticle.right_handedness
    name = "AntiPhoton"

class Graviton(Photon):
    name = "Graviton"

    def getHelix(self):
        """
        Photon isn't a helix...
        """
        photon_wave = Photon().getHelix()
        antiphoton_wave = AntiPhoton().getHelix()

        combined_wave = np.append(photon_wave, antiphoton_wave,axis=0)

        return combined_wave


class Neutrino(Gen1,ElementaryParticle):
    coilHandedness = ElementaryParticle.left_handedness
    quanta=1
    windings=1
    totalWindings=1
    name = "Neutrino"

    def getHelix(self):
        """
        Neutrino isn't a helix...
        """
        r = Neutrino.spinRadius
        t = np.arange(-np.pi, np.pi, 0.1)
        x = r * np.sin(t)
        y = self.coilHandedness*r * np.cos(t)
        z = self.amplitude*r * np.sin(self.period*t)

        return np.stack([x, y, z],axis=1)

class AntiNeutrino(Neutrino):
    coilHandedness = ElementaryParticle.right_handedness
    name = "AntiNeutrino"

class MuonNeutrino(Gen2,Neutrino):
    name = "MuonNeutrino"


class MuonAntiNeutrino(MuonNeutrino):
    coilHandedness = ElementaryParticle.right_handedness
    name = "MuonAntiNeutrino"

class TauNeutrino(Gen3,Neutrino):
    name = "TauNeutrino"

class TauAntiNeutrino(TauNeutrino):
    coilHandedness = ElementaryParticle.right_handedness
    name = "TauAntiNeutrino"

class Electron(ClosedTorus):
    coilHandedness = ElementaryParticle.left_handedness
    name = "Electron"

class Positron(Electron):
    coilHandedness = ElementaryParticle.right_handedness
    name = "Positron"

class Muon(Gen2,ClosedTorus):
    coilHandedness = ElementaryParticle.left_handedness
    name = "Muon"

class AntiMuon(Muon):
    coilHandedness = ElementaryParticle.right_handedness

class Tau(Gen3,ClosedTorus):
    coilHandedness = ElementaryParticle.left_handedness
    name = "Tau"

class AntiTau(Tau):
    coilHandedness = ElementaryParticle.right_handedness
    name = "AntiTau"

class Wminus(OpenTorus):
    coilHandedness = ElementaryParticle.left_handedness
    name = "Wminus"

class Wplus(Wminus):
    coilHandedness = ElementaryParticle.right_handedness
    name = "Wplus"

class Up(TwoThirdsTorus):
    coilHandedness = ElementaryParticle.right_handedness
    name = "Up"

class AntiUp(Up):
    coilHandedness = ElementaryParticle.left_handedness
    name = "AntiUp"

class Down(OneThirdTorus):
    coilHandedness = ElementaryParticle.left_handedness
    name = "Down"

class AntiDown(Down):
    coilHandedness = ElementaryParticle.right_handedness
    name = "AntiDown"

class Charm(Gen2,TwoThirdsTorus):
    coilHandedness = ElementaryParticle.right_handedness
    name = "Charm"

class AntiCharm(Charm):
    coilHandedness = ElementaryParticle.left_handedness
    name = "AntiCharm"

class Strange(Gen2,OneThirdTorus):
    coilHandedness = ElementaryParticle.left_handedness
    name = "Strange"

class AntiStrange(Strange):
    coilHandedness = ElementaryParticle.right_handedness
    name = "AntiStrange"

class Top(Gen3,TwoThirdsTorus):
    coilHandedness = ElementaryParticle.right_handedness
    name = "Top"

class AntiTop(Top):
    coilHandedness = ElementaryParticle.left_handedness
    name = "AntiTop"

class Bottom(Gen3,OneThirdTorus):
    coilHandedness = ElementaryParticle.left_handedness
    name = "Bottom"

class AntiBottom(Bottom):
    coilHandedness = ElementaryParticle.right_handedness
    name = "AntiBottom"

class Gluon(ElementaryParticle):
    coilHandedness=0
    windings=1/2
    quanta=1
    name="Gluon"
    particleA=False
    particleB=False
    particleA_end=0
    particleB_end=0

    def __init__(self,
                 particleA:HelixParticle=False,
                 particleB:HelixParticle=False,
                 particleA_end=1, #By default particles as oriented strings are joined from coil start to coil end.
                 particleB_end=0,
                 ):
        self.particleA=particleA
        self.particleB=particleB
        self.particleA_end=particleA_end
        self.particleB_end=particleB_end
        super().__init__()

    def getGluonHalf(self,particle:HelixParticle,end):
        """
        Return one half of gluon based on particle.
        If end parameter is specified (1 or 0) gluon half is attached to either end (1) or start (0) of particle helix
        """
        winding_length = (2*np.pi)/particle.totalWindings

        #Compute how much space is left for gluon from 1/3 or 2/3 of a circle after adding particle
        arc_space = round((particle.windings/particle.totalWindings) * 3) / 3  #1/3 or 2/3 how much space should particle + gluon take
        remaining_space = arc_space-particle.windings/particle.totalWindings #Space remaining for gluon after particle
        gluon_total_windings = 1/remaining_space #The correspoinding pitch for gluon half, results always 1/3->210 and 2/3 -> 105

        if end:
            arc_length=particle.windings * winding_length*particle.coilHandedness #Arc length in radians

            gluon_start=arc_length+particle.getMajorOrientation()
            gluon_minor_orientation = particle.getMinorOrientation()
        else:
            before_length = self.windings*(2*np.pi/gluon_total_windings)*particle.coilHandedness

            gluon_start=particle.getMajorOrientation()-before_length
            gluon_minor_orientation=np.pi+particle.getMinorOrientation()

        gluon_points = helix_along_circle(
            arc_windings=self.windings,
            total_windings=gluon_total_windings, # Gluon attached to particle should have same helix pitch so that it exactly fills remaining space from 1/3 or 2/3 of particle arc?
            major_radius=particle.torusRadius,
            minor_radius=particle.helixRadius,
            coil_handedness=particle.coilHandedness,
            # ADDED
            annihilation_pitch=particle.annihilationPitch,
            major_start=gluon_start, #start
            minor_start=gluon_minor_orientation,
            num_quanta=self.quanta/2
            )

        # Fit points to a triangle plane and move center to center of triangle
        #if particle.position:
        #    gluon_points = fit_curve_to_position(particle.position, gluon_points)
        if particle.position:
            if particle.annihilationPitch == 0:
                gluon_points = fit_curve_to_position(particle.position, gluon_points)
            else:
                if end:
                    particle.position.origin=particle.position.origin+np.array([0,0,0])
                else:
                    if particle.windings == 46:
                        particle.position.origin=particle.position.origin+np.array([0,0,2*particle.annihilationPitch/3])
                    if particle.windings == 92:
                        particle.position.origin=particle.position.origin+np.array([0,0,-4*particle.annihilationPitch/3])
                gluon_points = fit_curve_to_position(particle.position, gluon_points)

        return gluon_points


    def getGluonWithoutParticle(self):
        """
        Returns S-shaped gluon not attached to any particle
        """
        r = ElementaryParticle.spinRadius
        plot_resolution = 0.1

        xa=r*np.sin(np.arange(-np.pi, 0, plot_resolution))
        ya=r*np.cos(np.arange(-np.pi,0,plot_resolution))-r
        za = np.zeros(len(xa))


        a=np.stack([xa,ya,za],axis=1)


        xb=r*np.sin(np.arange(0, np.pi, plot_resolution))
        yb=r*np.cos(np.arange(0,np.pi,plot_resolution))*-1+r
        zb = np.zeros(len(xb))
        b=np.stack([xb,yb,zb],axis=1)

        return a,b


    def getHelix(self):
        """
        If gluon is not attached to any other particle, return straight S-curve.
        If gluon is attached to particles A and B the two halves of S should be last segments of particle A and B helixes forming an S with an angle in the middle
        """

        if self.particleA and self.particleB:
            a=self.getGluonHalf(self.particleA,self.particleA_end)
            b=self.getGluonHalf(self.particleB,self.particleB_end)
        else:
            a,b=self.getGluonWithoutParticle()

        return np.append(a,b,axis=0)

class AntiGluon(Gluon):
    """
    AntiGluon class that inherits from Gluon and swaps the orientation of its helix.
    """
    name = "AntiGluon"

    def getGluonWithoutParticle(self):
        a,b = super().getGluonWithoutParticle()
        a[:, 1] *= -1
        b[:, 1] *= -1
        return a,b

In [5]:
#@title COMPLEX PARTICLE CLASSES
#ComplexParticleN classes provide methods for getting sides and gluons of complex particle composed of N quarks.
#TetraParticle and ClosedTetraParticle provide shared quark positioning logic in tetrahedron shaped particles (vector mesons, baryons, tetra-, hexa- and octa quarks)
from math import isclose


class ComplexParticle2():
    gluon_count=1

    def getSides(self):
        return self.sides

    def getGluons(self):
        if self.gluons:
          return self.gluons
        return []

    def getGluonAB(self):
        return self.gluons[0]

    def getSideAHelix(self):
        return self.sides[0].getHelix()

    def getSideBHelix(self):
        return self.sides[1].getHelix()

    def getGluonABHelix(self):
        return self.getGluonAB.getHelix()
    def _init_gluons(self):
        #Create gluons between each tetrahedron side
        r=range(0,self.gluon_count)
        self.gluons=[Gluon(particleA=self.sides[i%len(self.sides)],particleB=self.sides[(i+r.step)%len(self.sides)]) for i in r]


class ComplexParticle3(ComplexParticle2):

    def getGluonCA(self):
        return self.gluons[1]

    def getGluonBC(self):
        return self.gluons[2]

    def getSideCHelix(self):
        return self.sides[2].getHelix()

    def getGluonCAHelix(self):
        return self.getGluonCA.getHelix()

    def getGluonBCHelix(self):
        return self.getGluonBC.getHelix()


class ComplexParticle4(ComplexParticle3):

    def getSideDHelix(self):
        return self.sides[3].getHelix()

    def getGluonBD(self):
        return self.gluons[1]

    def getGluonDC(self):
        return self.gluons[2]
    def getGluonBDHelix(self):
        return self.getGluonBD.getHelix()

    def getGluonDCHelix(self):
        return self.getGluonDC.getHelix()

class ComplexParticle6(ComplexParticle4):

    def getSideEHelix(self):
        return self.sides[4].getHelix()

    def getSideFHelix(self):
        return self.sides[5].getHelix()
    def getGluonDE(self):
        return self.gluons[3]

    def getGluonEF(self):
        return self.gluons[4]

    def getGluonFA(self):
        return self.gluons[5]


    def getSideEHelix(self):
        return self.sides[4].getHelix()

    def getSideFHelix(self):
        return self.sides[5].getHelix()

    def getGluonEFHelix(self):
        return self.getGluonEF.getHelix()

    def getGluonFAHelix(self):
        return self.getGluonFA.getHelix()

class ComplexParticle8(ComplexParticle6):

    def getSideGHelix(self):
        return self.sides[6].getHelix()

    def getSideHHelix(self):
        return self.sides[7].getHelix()

    def getGluonFH(self):
        return self.gluons[5]

    def getGluonHG(self):
        return self.gluons[6]

    def getGluonGA(self):
        return self.gluons[7]


    def getSideGHelix(self):
        return self.sides[6].getHelix()

    def getSideHHelix(self):
        return self.sides[7].getHelix()


    def getGluonFHHelix(self):
        return self.getGluonFH.getHelix()

    def getGluonHGHelix(self):
        return self.getGluonHG.getHelix()

    def getGluonGAHelix(self):
        return self.getGluonGA.getHelix()

class TetraParticle():

    triangles = False,
    opposing_corners = False,
    centers=False,
    sides=False

    mode_normal = 0
    mode_prime = 2
    mode_star = 1

    tetraMinorOrientation = (np.pi+np.arccos(1/3))/2

    def __init__(self, sides,sequence,mode=mode_normal):
        self.sides=sides
        self.sequence=sequence

        tetra = TetraParticle.getScaledTetrahedron()
        points,triangles,centers,opposing_corners = TetraParticle.getTetrahedronData(*tetra)
        self.triangles=triangles
        self.centers=centers
        self.opposing_corners=opposing_corners
        self.points=points

        self._init_gluons()
        self.setMode(mode)

    def reverse_sequence(seq):
        """
        Reverses a circular sequence keeping first item same.
        """
        return [seq[0]]+seq[1:][::-1]

    def setMode(self,mode):
        if mode==TetraParticle.mode_star:
            self.flipSides=set([1,2])
        elif mode==TetraParticle.mode_prime:
            self.flipSides=set([2])
        else:
            self.flipSides=set()
        self._set_particle_sequence()

    def getModeTriangles(self):
        def f(i):
            if i in self.flipSides:
                return self.flipTriangle(i)
            return self.triangles[i]
        return [f(i) for i in range(len(self.triangles))]


    def scaleTetrahedron(a,b,c,d):
        """
        Scale tetrahedron so that helix coils on two neighbouring sides meet.
        """
        center = (a + b + c) / 3
        side_center_ab = (a + b) / 2
        distance_ab = np.linalg.norm(center - side_center_ab) #Distance from middle of tetrahedron edge to center.

        angle_sides = np.arccos(1/3) #Angle between two tetrahedron sides
        dist=(np.sqrt(2)*ElementaryParticle.spinRadius)/np.sqrt(1-np.cos(angle_sides)) #Compute how much bigger tetrahedron side has to be than helix, so that the sides of 2 helixes touch exactly
        ts = (HelixParticle.torusRadius+dist)/distance_ab

        a *=  ts
        b *=  ts
        c *=  ts
        d *=  ts

        return a,b,c,d

    def centerTetrahedron(a,b,c,d):
        """
        Move tetrahedron so that center is at (0,0,0)
        """
        center = (a + b + c) / 3
        a-=center
        b-=center
        c-=center
        d-=center

        return a,b,c,d

    def createTetrahedron():
        a = np.array([0., 0., 0.])
        b = np.array([1., 0., 0.])
        c = np.array([0.5, np.sqrt(3)/2, 0.])
        d = np.array([0.5, np.sqrt(3)/6, np.sqrt(2/3)])

        return a,b,c,d

    def getTetrahedronData(a,b,c,d):
        ta = np.array([a, c, b])
        tb = np.array([a, b, d])
        tc = np.array([a, d, c])
        td = np.array([b, c, d])

        triangles = np.array([ta,tb,tc,td])
        opposite_corners = np.array([d,c,b,a]) #corners not part of triangles
        centers = np.sum(triangles,axis=1)/3
        points = [a,b,c,d]
        return points, triangles, centers,opposite_corners

    def getScaledTetrahedron():
        tetra=TetraParticle.createTetrahedron() #Create regular tetrahedron
        tetra=TetraParticle.centerTetrahedron(*tetra) #Center tetrahedron to (0,0,0)
        tetra=TetraParticle.scaleTetrahedron(*tetra) #Scale tetrahedron so that helix curves on neighbouring sides meet.

        return tetra

    def flipTriangle(self,side_index):
        triangle = self.triangles[side_index]
        delta = self.points[0]-self.centers[3]
        adjustement = 2 * (ElementaryParticle.spinRadius-9/ClosedTetraParticle.totalWindings*np.pi) * delta / np.linalg.norm(delta)

        #A small adjustment from Gluon alignment printout to make gluon half ends meet exactly
        adjustement=adjustement/np.linalg.norm(adjustement)*1.6329931618554503
        ####
        delta -= adjustement
        new_apex=self.centers[3]-adjustement
        t = pop_rows_by_value(triangle,[self.points[0]])
        t+=delta
        nt = np.append(t,[new_apex],axis=0)
        return nt

    def swapSide(self,side_i:int,particle:HelixParticle):
        """
        Replaces a side with another quark. Can't be used to set initial quarks.
        """

        old_pos=self.sides[side_i].position

        # if arc lengths and coil handednesses are same, do nothing. If different multiply minorOrientation and rotation vector by -1
        qar = ClosedTetraParticle._quark_arc_route(particle)*ClosedTetraParticle._quark_arc_route(self.sides[side_i])
        ch = particle.coilHandedness*self.sides[side_i].coilHandedness

        pp=ParticlePosition(
                origin=old_pos.origin,
                rotationVector=old_pos.rotationVector*qar,
                normalVector=old_pos.normalVector,
                anchor=ParticlePosition.anchor_opening,
                minorOrientation=old_pos.minorOrientation*ch,
                anchor_gluon=0,
            )
        particle.setParticlePosition(pp)
        self.sides[side_i]=particle


    def _quark_arc_route(p):
        """
        returns -1 for particles 1/3 arc length and 1 for particles with 2/3 arc length
        """
        arc_length=((p.windings+1)/p.totalWindings)
        tol = 1/p.totalWindings
        if isclose(arc_length, 1/3,abs_tol=tol):#Particle is 1/3 full circle +/- gluons
            rot=-1 #Point towards common corner
        elif isclose(arc_length, 2/3, abs_tol=tol):
            rot=1 #Point away from common corner
        return rot


    def _set_particle_sequence(self):
        """
        particles: list of particles to include in tetrahedron in order
        sequence: sequence of tetrahedron sides where particles should be inserted. sides are numbered 0,1,2,3
        In tetrahedron a,b,c,d where a,b,c is base and d is peak.
            0: base of tetrahedron (a,b,c)
            running clockwise around base
            1: side (a,b,d)
            2: side (a,c,d)
            3: side (b,c,d)


        particle is positioned to center of tetrahedron side
        particle opening is always pointed towards the corner that is between particle arc start and end or directly away from this corner depending on arc length.
        normal vector  is pointed towards opposing corner of tetrahedron
        """

        for i,p in enumerate(self.sides):

            side_index = self.sequence[i]

            prev_index = self.sequence[(i-1)%len(self.sequence)]
            next_index = self.sequence[(i+1)%len(self.sequence)]

            mo=self.tetraMinorOrientation

            #Common corner is the corner between start and end of quark.
            common_corner= intersect_2d_arrays(self.triangles[prev_index],self.triangles[side_index],self.triangles[next_index])[0]

            if side_index in self.flipSides:

                nt = self.flipTriangle(side_index)
                origin =  np.mean(nt, axis=0)
                rv=nt[-1]-origin
                nv= np.cross(nt[1]-origin,nt[0]-origin)
                mo*=-1

            else:
                rv=(common_corner-self.centers[side_index])
                nv=(self.opposing_corners[side_index]-self.centers[side_index])
                origin =self.centers[side_index]


            #If quark has 1/3 length arc should point towards rotation vector, if 2/3 away.
            rv*=ClosedTetraParticle._quark_arc_route(p)

            pp=ParticlePosition(
                origin=origin,
                rotationVector=rv,
                normalVector=nv,
                anchor=ParticlePosition.anchor_opening,
                minorOrientation=mo*p.coilHandedness,
                anchor_gluon=0,
            )
            p.setParticlePosition(pp)


class OpenTetraParticle(TetraParticle):
    totalWindings=139
    def __init__(self, sides,sequence, mode=TetraParticle.mode_normal):
        for p in sides:
            p.setTotalWindings(self.totalWindings)
        self.gluon_count=len(sides)-1
        super().__init__(sides=sides, sequence=sequence, mode=mode)

class ClosedTetraParticle(TetraParticle):
    totalWindings=140

    def __init__(self, sides,sequence, mode=TetraParticle.mode_normal):
        for p in sides:
            p.setTotalWindings(self.totalWindings)
        #if sequence starts with antiquark, it needs to be reversed
        if not sides[0].isQuark():
            sequence = TetraParticle.reverse_sequence(sequence)
        self.gluon_count=len(sides)
        super().__init__(sides=sides, sequence=sequence, mode=mode)

In [6]:
#@title BARYONS
class Baryon(ComplexParticle3, ClosedTetraParticle):
    """
    Tetrahedron shaped particle composed of tree helixes
    """

    def __init__(self, side_a: HelixParticle, side_b: HelixParticle, side_c: HelixParticle, mode=TetraParticle.mode_normal):
        """
        Create a baryon with given helixes
        """
        super().__init__(sides=[side_a,side_b,side_c],sequence=[0,2,1],mode=mode)

class Proton(Baryon):
    def __init__(self):
        return super().__init__(Down(),Up(),Up())

class Neutron(Baryon):
    def __init__(self):
        return super().__init__(Up(),Down(),Down())

class Lambda_(Baryon):
    def __init__(self):
        return super().__init__(Down(),Down(),Down())

class LambdaPlusPlus(Baryon):
    def __init__(self):
        return super().__init__(Up(),Up(),Up())

In [7]:
#@title MESONS
class PseudoscalarMeson(ComplexParticle2):
    """
    Two triangles edge-to-ege (kite) in the same plane house a quark and anti-quark and a superposition of Up, and AntiUp as well as Down and AntiDown known as the pi0 in the antisymmetric combination and sigma in the symmetric combination.
    """
    #When quark is added to meson, it's coil is condensed to make room for one gluon keeping same arc length (1/3 or 2/3 of circle)
    totalWindings=139
    def __init__(self, side_a: HelixParticle, side_b: HelixParticle,sup=False):
        """
        Initialize the particles that form sides of meson

        Pseudoscalar meson is composed of two quarks, joined end to start. this is done so that the join with gluon is located at 0,0,0
        """
        side_a.setTotalWindings(self.totalWindings)
        side_b.setTotalWindings(self.totalWindings)
        self.reverse=sup
        if sup:
            rot=-1
        else:
            rot=1

        pa=ParticlePosition(
            origin=np.array([0,-HelixParticle.torusRadius-ElementaryParticle.spinRadius,0]),
            normalVector=np.array([0,0,1]),
            rotationVector=np.array([0,-1,0]),
            anchor=ParticlePosition.anchor_end*rot,
            minorOrientation=np.pi,
            anchor_gluon=1
        )

        pb=ParticlePosition(
            origin=np.array([0,HelixParticle.torusRadius+ElementaryParticle.spinRadius,0]),
            normalVector=np.array([0,0,1]),
            rotationVector=np.array([0,1,0]),
            anchor=ParticlePosition.anchor_start*rot,
            minorOrientation=np.pi,
            anchor_gluon=1
        )

        side_a.setParticlePosition(pa)
        side_b.setParticlePosition(pb)

        if sup:
          self.sides=[side_b,side_a]
        else:
          self.sides=[side_a,side_b]
        self._init_gluons()

        # Inside your PseudoscalarMeson class

    def reset_gluons(self):
        """
        Reinitialize the gluons after modifying the positions of quark and antiquark.
        """
        self._init_gluons()  # Assuming _init_gluons handles proper setup


class PionMinus(PseudoscalarMeson):
    def __init__(self):
        return super().__init__(Down(),AntiUp())

class PionPlus(PseudoscalarMeson):
    def __init__(self):
        return super().__init__(Up(),AntiDown())

class PionUAU(PseudoscalarMeson):
    def __init__(self):
        return super().__init__(Up(),AntiUp())

class PionDAD(PseudoscalarMeson):
    def __init__(self):
        return super().__init__(Down(),AntiDown())

class PionADD(PseudoscalarMeson):
    def __init__(self):
        return super().__init__(AntiDown(),Down(),sup=True)

class PionADD2(PseudoscalarMeson):
    def __init__(self):
        return super().__init__(AntiDown(),Down(),sup=False)

class PionDAD2(PseudoscalarMeson):
    def __init__(self):
        return super().__init__(AntiDown(),Down(),sup=True)

class K0(PseudoscalarMeson):
    def __init__(self):
        return super().__init__(Down(),AntiStrange())

class AntiK0(PseudoscalarMeson):
    def __init__(self):
        return super().__init__(Strange(),AntiDown())

class D0(PseudoscalarMeson):
    def __init__(self):
        return super().__init__(Charm(),AntiUp())

class AntiD0(PseudoscalarMeson):
    def __init__(self):
        return super().__init__(Up(),AntiCharm())

class TestMesonSAD(PseudoscalarMeson):
    def __init__(self):
        return super().__init__(Strange(),AntiDown())

class TestMesonDAS(PseudoscalarMeson):
    def __init__(self):
        return super().__init__(Down(),AntiStrange())

class TestMesonASD(PseudoscalarMeson):
    def __init__(self):
        return self.__init_pseudoscalar_reverse__(AntiStrange(),Down())

class TestMesonUAU(PseudoscalarMeson):
    def __init__(self):
        return super().__init__(Up(),AntiUp())

class TestMesonDAD(PseudoscalarMeson):
    def __init__(self):
        return super().__init__(Down(),AntiDown())

class TestMesonADD(PseudoscalarMeson):
    def __init__(self):
        return self.__init_pseudoscalar_reverse__(AntiDown(),Down())

class TestMesonUAD(PseudoscalarMeson):
    def __init__(self):
        return super().__init__(Up(),AntiDown())

class TestMesonDAU(PseudoscalarMeson):
    def __init__(self):
        return super().__init__(Down(),AntiUp())

class KaonDAS(PseudoscalarMeson):
    def __init__(self):
        return super().__init__(Down(),AntiStrange())

class KaonADS(PseudoscalarMeson):
    def __init__(self):
        return super().__init__(Strange(),AntiDown())


class VectorMeson(ComplexParticle2,OpenTetraParticle):
    """
    Tetrahedron shaped particle composed of two helixes corresponding to a quark-antiquark pair on adjacent tetrahedron faces

    """

    def __init__(self,side_a:HelixParticle,side_b:HelixParticle,sup=False):
        """
        For opent tetrahedron particles (ie. particles don't form a closed loop) it is necessary to define sequence for the side quarks + where the quark sequence shoudl continue at end and start
        """

        sequence = [0,1,2,3]
        if sup:
          sequence = [1,0,3,2]
        if not side_a.isQuark():
          sequence=[0,1,3,2]
          if sup:
            sequence = [1,0,2,3]

        super().__init__(sides=[side_a,side_b],sequence=sequence,mode=TetraParticle.mode_normal)
        # if sup:
        #     self.sides[0].position.normalVector*=-1
        #     self.sides[1].position.normalVector*=-1

class RhoMinus(VectorMeson):
    def __init__(self):
        return super().__init__(Down(),AntiUp())

class RhoPlus(VectorMeson):
    def __init__(self):
        return super().__init__(Up(),AntiDown())

class RhoUAU(VectorMeson):
    def __init__(self):
        return super().__init__(Up(),AntiUp())

class RhoADD(VectorMeson):
    def __init__(self):
        return super().__init__(AntiDown(),Down())

class RhoDAD(VectorMeson):
    def __init__(self):
        return super().__init__(Down(),AntiDown())

In [8]:
#@title EXOTIC MESONS
class TetraQuark(ComplexParticle4, ClosedTetraParticle):

    """
    Tetrahedron shaped particle composed of four helixes quark-antiquark pairs

    All closed loop tetrahedron particles (baryons, tetraquarks, hexaquarks, octaquarks) can use same logic for plotting. (implemented in ClosedTetraParticle class)
    """
    def __init__(self, side_a: HelixParticle, side_b: HelixParticle, side_c: HelixParticle, side_d: HelixParticle):
        """
        Create a tetraquark with given helixes
        """

        super().__init__(sides=[side_a,side_b,side_c,side_d],sequence=[0,2,3,1])

class TestPrtonLike(TetraQuark):
    def __init__(self):
        super().__init__(Down(),Up(),Strange(),Up())

# Examples
class TestTetraDADSAS(TetraQuark):
    def __init__(self):
        return super().__init__(Down(),AntiDown(),Strange(),AntiStrange())

class TestTetraUAUDAD(TetraQuark):
    def __init__(self):
        return super().__init__(Up(),AntiUp(),Down(),AntiDown())

class TestTetraUAUUAU(TetraQuark):
    def __init__(self):
        return super().__init__(Up(),AntiUp(),Up(),AntiUp())

class TestTetraAUUAUU(TetraQuark):  # A sequence starting with an antiquark is not implemented.
    def __init__(self):

        return super().__init__(AntiUp(),Up(),AntiUp(),Up()) #For this to work just need to communicate to _init_ to not reverse gluons.


class HexaQuark(ComplexParticle6,ClosedTetraParticle):
    """
    Tetrahedron shaped particle composed of six helixes
    """
    def __init__(self, side_a: HelixParticle, side_b: HelixParticle, side_c: HelixParticle, side_d: HelixParticle, side_e: HelixParticle, side_f: HelixParticle,mode=TetraParticle.mode_normal):
        """
        Create a hexaquark with given helixes
        """
        super().__init__(sides=[side_a,side_b,side_c,side_d,side_e,side_f],sequence=[0,2,1,0,2,1],mode=mode)

class UUUDDD(HexaQuark):
    def __init__(self):
        return super().__init__(Up(),Up(),Up(),Down(),Down(),Down())

class UDDADAUAU(HexaQuark):
    def __init__(self):
        return super().__init__(Up(),Down(),Down(),AntiDown(),AntiUp(),AntiUp())


class OctaQuark(ComplexParticle8,ClosedTetraParticle):
    """
    Tetrahedron shaped particle composed of eight helixes of quark-antiquark pairs    """

    def __init__(self, side_a: HelixParticle, side_b: HelixParticle, side_c: HelixParticle, side_d: HelixParticle, side_e: HelixParticle, side_f: HelixParticle, side_g: HelixParticle, side_h: HelixParticle):
        """
        Create a octaquark with given helixes
        """
        super().__init__(sides=[side_a,side_b,side_c,side_d,side_e,side_f,side_g,side_h], sequence=[0,2,3,1,0,2,3,1])



class TestOctaUAUCACDADSAS(OctaQuark):
    def __init__(self):
        return super().__init__(Up(),AntiUp(),Charm(),AntiCharm(),Down(),AntiDown(),Strange(),AntiStrange())

class Higgs(OctaQuark):
    def __init__(self):
        return super().__init__(Up(),AntiUp(),Up(),AntiUp(),Down(),AntiDown(),Down(),AntiDown())

In [9]:
#@title PLOT PARTICLES
import plotly.graph_objects as go

class ParticlePlotter():

    particle_colors = {
      ElementaryParticle.left_handedness:["blue","purple","green"],
      ElementaryParticle.right_handedness:["red","orange","#C8C800"], #Vaihdettu keltainen vähemmän räikeään sävyyn.
    }

    def get_particle_color(p:ElementaryParticle):
      try:
        return ParticlePlotter.particle_colors[p.coilHandedness][p.coilGeneration-1]
      except:
        return "black"

    #In animations how long should a frame be displayed (33ms -> 30 frames per second)
    frame_duration = 33


    particle_line_width={'Gluon':4,'AntiGluon': 4}
    cone_scale_small=.1
    cone_scale_medium=.5
    cone_scale_large=1

    def add_trace_safe(*args,**kwargs):
      """
      Don't allow passing row or col if no subplot
      """
      fig = args[0]
      if  kwargs.get("col")==0 or kwargs.get("row")==0:
        kwargs.pop("col")
        kwargs.pop("row")
      fig.add_trace(*args[1:],**kwargs)


    def get_cones_for_curve(curve,cone_indices=np.array([-1])):
      """
      Generate cone objects to indicate direction along a 3D curve.

      Parameters:
      ----------
      curve : numpy.ndarray
          A 2D numpy array of shape (n, 3), where each row represents a point on the curve,
          with columns corresponding to the x, y, and z coordinates respectively.

      cone_indices : int, default -1
          Curve indices at which to place cones.

      offset : int, optional, default=0
          An index offset for starting the placement of cones along the curve.
          To place cones at specific position along helix minor axis use plot_resolution.

      Returns:
      -------
      cones : list of dict
          A list of cone dictionaries containing:
          - `x`, `y`, `z`: Coordinates for cone placement.
          - `u`, `v`, `w`: Direction vectors for each cone.

      Notes:
      -----
      - The function computes the tangent vectors along the curve to orient the cones.
      - Ensure that the input `curve` contains sufficient points to accurately compute directions.
      """

      if len(curve)<=1:
        return [[] for i in range(6)]


      x,y,z = curve.T

      # Compute direction vectors for arrows
      v = np.gradient(curve,axis=0)
      v=v/np.linalg.norm(v,axis=1)[:, np.newaxis]

      dx,dy,dz=v.T


      return [a[cone_indices] for a in [x,y,z,dx,dy,dz]]



    def addComplexParticleToPlot(complex: ComplexParticle2, fig, row=0, col=0,minor_axis_arc=True):
        """
        Add a vector meson to a plotly figure
        """
        for particle in complex.sides:
            if particle:
                ParticlePlotter.addParticleToPlot(particle, fig, row=row, col=col, minor_axis_arc=minor_axis_arc)

        for gluon in complex.getGluons():
            if gluon:
                ParticlePlotter.addParticleToPlot(gluon, fig, row=row, col=col,line={'color':ParticlePlotter.get_particle_color(gluon),'width': ParticlePlotter.particle_line_width.get(gluon.name) or 1},minor_axis_arc=False)


    def addConesToFig(cones, fig,row=0,col=0,color="black",scale=cone_scale_small):
        x,y,z,u,v,w = cones
        c = go.Cone(
          x=x,
          y=y,
          z=z,
          u=u,
          v=v,
          w=w,
          sizemode='raw',
          sizeref=scale,
          anchor='tip',
          colorscale= [[0, color], [1,color]],
          name='Direction',
          showscale=False
        )
        ParticlePlotter.add_trace_safe(fig, c,row=row, col=col)


    def addPhotonToPlot(photon:Photon,fig,row=0,col=0, line={}, cones=True):
        for wave in photon.getHelix():
          x, y, z = zip(*wave)
          ParticlePlotter.add_trace_safe(fig,go.Scatter3d(x=x, y=y, z=z, mode='lines',name=photon.name, line={'color':ParticlePlotter.get_particle_color(photon),'width': ParticlePlotter.particle_line_width.get(photon.name) or 1}), row=row, col=col)
          cones = ParticlePlotter.get_cones_for_curve(wave,photon.getQuantaIndices())
          ParticlePlotter.addConesToFig(cones,fig,row=row,col=col,color=ParticlePlotter.particle_colors[photon.coilHandedness])


    def addParticleToPlot(particle: HelixParticle, fig, row=0, col=0, line={},cones=True,minor_axis_arc=False,normalVector=False):
        """
        Add a helix to a plotly figure
        """
        #Particle curve
        helix = particle.getHelix()

        x, y, z = zip(*helix)
        ParticlePlotter.add_trace_safe(fig,go.Scatter3d(x=x, y=y, z=z, mode='lines',name=particle.name, line={'color':ParticlePlotter.get_particle_color(particle),'width': ParticlePlotter.particle_line_width.get(particle.name) or 1}), row=row, col=col)

        if cones:
          #Direction cones
          cones = ParticlePlotter.get_cones_for_curve(helix,particle.getQuantaIndices())
          ParticlePlotter.addConesToFig(cones,fig,row=row,col=col,color=ParticlePlotter.get_particle_color(particle))
        if minor_axis_arc:
          #Minor axis arc
          arc=particle.getMinorAxisArc()
          if arc.any():
            x,y,z=zip(*arc)
            ParticlePlotter.add_trace_safe(fig,go.Scatter3d(x=x, y=y, z=z, mode='lines',name=particle.name, line={'color':ParticlePlotter.get_particle_color(particle),}), row=row, col=col)
            cones = ParticlePlotter.get_cones_for_curve(arc)
            ParticlePlotter.addConesToFig(cones,fig,row=row,col=col,color=ParticlePlotter.get_particle_color(particle),scale=ParticlePlotter.cone_scale_medium)

        #NormalVector
        if normalVector:
          nv = particle.getNormalVector()
          if nv.any():
            torusCenter = particle.getTorusCenter()

            momentPlot = np.array([torusCenter,nv])
            x,y,z = zip(*momentPlot)
            ParticlePlotter.add_trace_safe(fig,go.Scatter3d(x=x, y=y, z=z, mode='lines',name=particle.name, line={'color':ParticlePlotter.get_particle_color(particle)}), row=row, col=col)

            x,y,z=nv
            u,v,w = (nv-torusCenter)/np.linalg.norm(nv-torusCenter)

            c = go.Cone(
              x=[x],
              y=[y],
              z=[z],
              u=[u],
              v=[v],
              w=[w],
              sizemode='raw',
              sizeref=ParticlePlotter.cone_scale_medium,  # Adjust the size of arrows
              anchor='tip',
              colorscale= [[0, ParticlePlotter.get_particle_color(particle)], [1,ParticlePlotter.get_particle_color(particle)]],
              name='Direction',
              showscale=False
            )
            ParticlePlotter.add_trace_safe(fig, c,row=row, col=col)

    def addTriangleStructureToPlot(structure,fig,row=0,col=0):

      structure = [np.append(triangle, [triangle[0]], axis=0) for triangle in structure]
      triangles = flatten_with_nan_delimiter(structure)
      x_t, y_t, z_t = zip(*triangles)
      ParticlePlotter.add_trace_safe(fig,go.Scatter3d(x=x_t, y=y_t, z=z_t, mode='lines',line_color="gray"), row=row, col=col)


    def animateParticleReaction(*particles,reaction_function:callable,fig):

        """
        Animates a a particle reaction.

        Args:
            *particles: A variable number of particle objects. Different reaction functions may expect different number of particles as arguments.
            reaction_function (callable): A function that takes particles as input and returns animation frame data. Returns a dict with particles as keys and their reaction frame data as values.
              -Reaction frame data is dict with key 'helix' containing helix shape and 'quanta_offset' telling how much quanta should be offset. quanta offset is used to keep whole quanta where quark changes to photons.
            fig (plotly.graph_objects.Figure): A Plotly figure object to render and update the animation. The figure should be set up with initial data for the particles that will be updated over time.

        Returns:
            None. The function directly updates the Plotly figure to animate the particles.

        Example:
            >>> animateParticleReaction(particle1, particle2, reaction_function=Reactions.annihilate, fig=fig)
        """

        particle_frames=reaction_function(*particles)

        frames=[]
        for i in range(len(particle_frames[particles[0]])):
          data=[]
          for particle, p_frame_data in particle_frames.items():
            p_frames=p_frame_data[i]['helix']
            if not p_frames.any():
              continue
            p_quanta_indices=particle.getQuantaIndices()
            p_quanta_indices-=p_frame_data[i]["quanta_offset"]
            xp,yp,zp,up,vp,wp= ParticlePlotter.get_cones_for_curve(p_frames,p_quanta_indices[p_quanta_indices<len(p_frames)])
            x,y,z=p_frames.T
            data.extend([
                  go.Scatter3d(
                  x =x,
                  y=y,
                  z=z,
                  mode='lines',
                  name="p",
                  line={'color':ParticlePlotter.get_particle_color(particle)}
                  ),
                  go.Cone(
                  x=xp,
                  y=yp,
                  z=zp,
                  u=up,
                  v=vp,
                  w=wp,
                  sizemode='raw',
                  sizeref=ParticlePlotter.cone_scale_small,  # Adjust the size of arrows to 1/20th of winding length
                  anchor='tip',
                  colorscale= [[0, ParticlePlotter.get_particle_color(particle)], [1,ParticlePlotter.get_particle_color(particle)]],
                  name='pcones',
                  showscale=False
                  ),

              ])


          frames.append(
            go.Frame(
            data= data,
              name=f'frame_{i}'

          )
          )


        fig.update(frames=frames,),

In [10]:
#@title TEST PLOTS
from plotly.subplots import make_subplots
fig = go.Figure()

#ParticlePlotter.addParticleToPlot(Wminus(),fig, coil_annihilation=True)
#ParticlePlotter.addComplexParticleToPlot(Proton(),fig)


#"UDDADAUAU"
#Onko yksi yhtenäinen ketju kvarkkeja vai ikäänkuin kaksi erillistä baryonia samassa tilassa?

#Kaksi erillistä osaa tulee nätisti
#ParticlePlotter.addComplexParticleToPlot(Baryon(Up(),Down(),Down()),fig)
#ParticlePlotter.addComplexParticleToPlot(Baryon(AntiDown(),AntiUp(),AntiUp()),fig)

#Kun yrittää plotata kaikki samassa hexakvarkissa gluonit ei toimi, mutta en oikein tajua miten ne voisikaan toimia.
#ParticlePlotter.addComplexParticleToPlot(UDDADAUAU(),fig)



p=Baryon(AntiDown(),AntiUp(),AntiUp())
p.setMode(TetraParticle.mode_prime)
ParticlePlotter.addComplexParticleToPlot(p,fig)
#ParticlePlotter.addParticleToPlot(AntiGluon(),fig)
#ParticlePlotter.addComplexParticleToPlot(UDDADAUAU(),fig)
#electron = Electron()
#electron.coilAnnihilation = True  # Flip coilAnnihilation to True
#ParticlePlotter.addParticleToPlot(electron, fig, minor_axis_arc=True)

#ParticlePlotter.addParticleToPlot(Muon(),fig)
#ParticlePlotter.addParticleToPlot(Tau(),fig)
#ParticlePlotter.addParticleToPlot(Wminus(),fig)
#ParticlePlotter.addParticleToPlot(Wplus(),fig)
#ParticlePlotter.addComplexParticleToPlot(PionMinus(),fig)
#ParticlePlotter.addComplexParticleToPlot(PionPlus(),fig)

# DEMO GLUON psmOFFSET PROBLEM. "Fixed" at psm class. Why do the two coils not overlay exactly when gluons do?
#ParticlePlotter.addComplexParticleToPlot(PionUAU(),fig)
#ParticlePlotter.addComplexParticleToPlot(PionADD2(),fig)

#ParticlePlotter.addComplexParticleToPlot(PionDAD2(),fig)
#ParticlePlotter.addComplexParticleToPlot(PionDAD(),fig)
#ParticlePlotter.addComplexParticleToPlot(PionADD(),fig)

#ParticlePlotter.addComplexParticleToPlot(VectorMeson(Up(),AntiUp(),sup=True),fig)
#ParticlePlotter.addComplexParticleToPlot(VectorMeson(Down(),AntiDown(),sup=False),fig)
#ParticlePlotter.addParticleToPlot(Neutrino(),fig)
#ParticlePlotter.addParticleToPlot(MuonNeutrino(),fig)
#ParticlePlotter.addParticleToPlot(TauNeutrino(),fig)



# Set some plot display options
plot_range = [-15, 15]

fig.update(layout_showlegend=False)
#fig.update_scenes(xaxis_visible=False, yaxis_visible=False, zaxis_visible=False)
fig.update_layout(scene = dict(xaxis=dict(range=plot_range, autorange=False),
                               yaxis=dict(range=plot_range, autorange=False),
                               zaxis=dict(range=plot_range, autorange=False),
                               )
                  )
fig.layout.scene.aspectratio = {'x':1, 'y':1, 'z':1}
fig.update_layout(
     width=800,  # Set figure width
     height=800,  # Set figure height to match width for square layout 4 subplots

)

# show plot
fig.show()

In [11]:
#@title PLOT LAYOUT
import numpy as np
import plotly.graph_objects as go
from scipy.spatial.transform import Rotation as R
from ipywidgets import Button, Layout, HBox, VBox, Output, Label
from IPython.display import display, HTML
class ParticleDemo:
  def apply_common_layout(self,fig):
      axes = 3 * (HelixParticle.torusRadius + ElementaryParticle.spinRadius + 1)
      axis_range = [-axes, axes]
      fig.update_layout(
          scene=dict(
              xaxis=dict(range=axis_range, visible=False),
              yaxis=dict(range=axis_range, visible=False),
              zaxis=dict(range=axis_range, visible=False),
              aspectmode="cube"),
          margin=dict(l=0, r=0, t=0, b=0),
          height=400, width=400,
          scene_camera=self.scene_camera or dict(eye=dict(x=0.5, y=0.5, z=0.3)),
          paper_bgcolor="white", plot_bgcolor="white", showlegend=False)

  def dummy_fig():
    return go.Figure().update_layout(
        width=50, height=50, xaxis_visible=False, yaxis_visible=False,
        scene=dict(xaxis=dict(visible=False), yaxis=dict(visible=False), zaxis=dict(visible=False)),
        margin=dict(l=0, r=0, t=0, b=0), paper_bgcolor='white', plot_bgcolor='white', showlegend=False)

  def update_figure(self,output, figure, quark, add_quark_func, show_fig=True):
      """
      Updates a given Plotly figure within the specified output widget without clearing it.

      Parameters:
      - output: The output widget to update.
      - figure: The Plotly figure to update.
      - quark: The quark to add to the plot (or None if no quark exists).
      - add_quark_func: Function to add the quark to the figure.
      - show_fig: A boolean parameter to determine whether to display the figure.
      """
      with output:
          if quark:
              add_quark_func(quark, figure)
              self.refigure_layout()
              if show_fig:
                  figure.show()

  def clear_figure(self, output, figure):
      """
      Clears and updates a given Plotly figure within the specified output widget.
      """
      with output:
          output.clear_output(wait=True)
          figure.data = []  # Clear previous plot
          self.refigure_layout()

  def clear_and_update_figure(self,output, figure, quark, add_quark_func):
    """
    Clears and updates a given Plotly figure within the specified output widget.

    Parameters:
    - output: The output widget to clear and update.
    - figure: The Plotly figure to update.
    - quark: The quark to add to the plot (or None if no quark exists).
    - add_quark_func: Function to add the quark to the figure.
    """
    self.clear_figure(output, figure)
    self.update_figure(output, figure, quark, add_quark_func, show_fig=True)

    # Define the dictionaries
  quarks = {
      'u': {'quark': Up, 'label': "u", 'color': "red"},
      'd': {'quark': Down, 'label': "d", 'color': "blue"},
      'c': {'quark': Charm, 'label': "c", 'color': "orange"},
      's': {'quark': Strange, 'label': "s", 'color': "purple"},
      't': {'quark': Top, 'label': "t", 'color': "yellow"},
      'b': {'quark': Bottom, 'label': "b", 'color': "green"}
  }


  antiquarks = {
      'au': {'antiquark': AntiUp, 'label': "u̅", 'color': "blue"},
      'ad': {'antiquark': AntiDown, 'label': "d̅", 'color': "red"},
      'ac': {'antiquark': AntiCharm, 'label': "c̅", 'color': "purple"},
      'as': {'antiquark': AntiStrange, 'label': "s̅", 'color': "orange"},
      'at': {'antiquark': AntiTop, 'label': "t̅", 'color': "green"},
      'ab': {'antiquark': AntiBottom, 'label': "b̅", 'color': "yellow"}
  }


  symbols = {
      'red':"🔴",
      'blue':"🔵",
      'orange':"🟠",
      'purple':"🟣",
      'yellow':"🟡",
      'green':"🟢",
  }

  columns_layout=Layout(align_items="center",width="410px")

  lbox_layout = Layout(justify_content="center", gap="20px",width="100%",height=f"{30}px")
  hbox_layout = Layout(justify_content="center", gap="20px",width="100%",height=f"{410}px")

  ui_layout = Layout(align_items="center", spacing="5px",width="100vw",height="")

  def display(self):
    # Display the UI
    display(HTML(f'<span style="color: gray; font-size: 20px;">{self.title}</span><br><br>'))
    display(self.ui)



In [12]:
#@title STRING MASS MODEL
"""
PARTICLE MASSES FROM THE QUANTUM OF ACTION
===========================================
Annila, E., & Annila, A. (2026). Particles and Vacuum as Strings from the
Quantum of Action. Zenodo. https://doi.org/10.5281/zenodo.18669551

Each particle mass = curvature cancellation + twist + excitation.

FUNDAMENTAL CONSTANTS
alpha = 1 / 137.036
me    = 0.511          # MeV
m10    = me * 137 / (138 * alpha)   # 69.518 MeV
mu    = me / 3         # 0.170 MeV

CURVATURE CANCELLATION OF QUARK AND ANTIQUARK IN
  pseudoscalar PLANAR CONFORMATION
  m1s0 : 1st–s   cancellation in singlet
  mss0 : s–s     cancellation
  m1c0 : 1st–c   cancellation in singlet
  msc0 : s–c     cancellation
  mcc0 : c–c     cancellation
  m1b0 : 1st–b   cancellation in singlet
  msb0 : s–b     cancellation
  mcb0 : c–b     cancellation
  mbb0 : b–b     cancellation

CURVATURE CANCELLATION OF QUARKS IN
  baryon AND vector meson TETRAHEDRAL CONFORMATION
  m11 : 1st–1st gen tetrahedral arc-pair, 23 non-canceling loops (= 312.5 MeV)
  m1s : 1st–s   cancellation in singlet
  mss : s–s     cancellation
  m1c : 1st–c   cancellation in singlet
  msc : s–c     cancellation
  mcc : c–c     cancellation
  m1b : 1st–b   cancellation in singlet
  msb : s–b     cancellation
  mcb : c–b     cancellation
  mbb : b–b     (from Υ/2)
  m1  : 1st gen terminus
  ms  : strange terminus
  mc  : charm terminus
  mb  : bottom terminus

TWIST OF QUARKS IN TETRAHEDRAL CONFORMATION OF baryons
  Twists of 2nd and 3rd generation quarks, propagating along the torus, cannot
  relax in a closed circulation but perturbs the neighboring quark at the gluon,
  hence the order of quarks matter.
  mfds : u/d before s  (76.9 MeV)
  mfcu : u/d before c  (166.4 MeV)
  mfdb : u/d before b  (193.8 MeV)
  mfsb : s before b    (143.1 MeV)
  mfcb : c before b    (31.5 MeV)
  mfdss: d before ss   (Ξ isospin split, 6.8 MeV)
  mf1sc: d or u in usc or dsc

EXCITATIONS
  SPIN FLIPS: One quark flips to the mirror tetrahedron face J=3/2, two J=5/2,
    etc., including various combinations and their time averaged states.
  mes : flip of s  (191.1 MeV)
  mec : flip of c  ( 64.6 MeV)
  meb : flip of b  ( 19.6 MeV)
  mes_ss :         (216.9 MeV)
  mes_sss :        (137.4 MeV)
  ORBITAL: The quark and antiquark rotate around each other with quantized
    angular momentum, not modeled.
  RADIAL: The quark–antiquark separation oscillates, not modeled.

TAGS
  !  singlet (antisymmetric, lowest twisted state)
  ^  prime (higher twisted state)
  *  J=3/2 excitation
  _bar  antiquark (meson)
  %  vector meson
"""

import numpy as np

# ── FUNDAMENTAL CONSTANTS ─────────────────────────────────────────
alpha = 1 / 137.036
me    = 0.511          # MeV
m10    = me * 137 / (138 * alpha)   # 69.518 MeV
mu    = me / 3         # 0.170 MeV

# ── TETRAHEDRON GEOMETRY (basic, tilt, flip) ──────────────────────────
def _norm(v): return v / np.linalg.norm(v)
def _rot(v, ax, a):
    ax = _norm(ax); vp = np.dot(v,ax)*ax; vn = v - vp
    return vp + vn*np.cos(a) + np.cross(ax,vn)*np.sin(a)
def _ang(u, v):
    return np.arccos(np.clip(np.dot(_norm(u),_norm(v)),-1,1))

a  = 1.0
V2 = np.array([ a/np.sqrt(3), 0, 0])
V3 = np.array([-a/(2*np.sqrt(3)),  a/2, 0])
V4 = np.array([-a/(2*np.sqrt(3)), -a/2, 0])
V1 = np.array([0, 0, np.sqrt(2/3)*a])

def _fn(A, B, C): return _norm(np.cross(B-A, C-A))
_n1 = _fn(V1,V2,V3);  _n2 = _fn(V1,V3,V4)
_t1 = _norm(np.cross(_n1, _norm(V3-V2)))
_t2 = _norm(np.cross(_n2, _norm(V4-V3)))

def _tilt(n, t, deg):
    ax = _norm(V3 - V2); a = np.radians(deg)
    return _rot(n,ax,a), _rot(t,ax,a)

def arc23(u, v, nu, nv, gluon=0.5, i1=30., i2=30.,
          t1d=0., t2d=0., r1=1, r2=1, ns=23):
    """23-step curvature accumulation between two arc tangents."""
    nu,u = _tilt(nu,u,t1d);  nv,v = _tilt(nv,v,t2d)
    pl = 2*np.pi/138;  off = gluon*pl
    u = _rot(u,nu, np.radians(i1)+off)
    v = _rot(v,nv,-np.radians(i2)-off)
    cum = 0.0
    for _ in range(ns):
        cum += 2*np.sin(_ang(u,v)/2)**2
        u = _rot(u,nu, pl*r1);  v = _rot(v,nv,-pl*r2)
    return m10 * cum

# ── DERIVED GEOMETRIC PARAMETERS ──────────────────────────────────
m11  = arc23(_t1.copy(),_t2.copy(),_n1,_n2)
# Resonance flip (J=3/2): quark on mirror face, both arcs forward (reversed sense)
m11r = arc23(_t1.copy(),_t2.copy(),_n1,_n2,
             i2=150., t2d=2*70.53, r2=-1)
# minor tilt
_tilt_s = arc23(_t1.copy(),_t2.copy(),_n1,_n2, t1d=-7.5)
_tilt_c = arc23(_t1.copy(),_t2.copy(),_n1,_n2, t1d=-2.5)
_tilt_b = arc23(_t1.copy(),_t2.copy(),_n1,_n2, t1d=-0.5)

# ── REFERENCE MASSES ──────────────────────────────────────────────
PDG = {
    # mesons
    'ud_bar':139.57, 'dd_bar':134.98, 'ud_bar%':775.26,
    'us_bar':493.70, 'ds_bar':497.61,
    'us_bar%':891.66, 'ds_bar%':895.55, 'ss_bar%':1019.46,
    'cu_bar':1864.84,'cd_bar':1869.70,'cs_bar':1968.34,'cc_bar':2983.90,
    'cu_bar%':2006.97,'cd_bar%':2010.26,'cs_bar%':2112.10,'cc_bar%':3096.90,
    'ub_bar':5279.34,'db_bar':5279.66,'sb_bar':5366.93,'cb_bar':6274.47,'bb_bar':9859.44,
    'ub_bar%':5324.70,'db_bar%':5324.71,'bb_bar%':9460.30,
    # 1st gen baryons
    'uud':938.30,'udd':939.60,'uuu*':1232.00,
    # strange
    'uds!':1115.70,'uds':1192.60,'uus':1189.40,'dds':1197.40,
    'uss':1314.90,'dss':1321.70,
    'uds*':1383.70,'uus*':1382.80,'dds*':1385.40,
    'uss*':1531.80,'dss*':1535.00,'sss*':1672.50,
    # charm
    'udc!':2286.50,'udc':2452.90,'uuc':2453.90,'ddc':2453.70,
    'udc*':2517.50,'uuc*':2518.40,'ddc*':2518.50,
    'usc!':2467.90,'dsc!':2470.90,
    'usc':2578.20,'dsc':2579.20,
    'usc*':2645.60,'dsc*':2646.40,
    'ssc':2695.20,'ssc*':2765.90,
    'ucc':3621.40,'dcc':3619.97,'scc':3738.00,
    'ucc*':3656.48,'dcc*':3656.48,'scc*':3750.00,
    # bottom
    'udb!':5619.60,'udb':5813.40,'uub':5810.60,'ddb':5815.60,
    'udb*':5833.00,'uub*':5830.30,'ddb*':5834.70,
    'usb!':5791.90,'dsb!':5797.00,
    'usb':5935.00,'dsb':5935.80,
    'ssb':6046.10,
    'ucb!':7005.75,'ucb':7037.24,
    # predicted
    'scb':7000,
    'ubb':10200,
    'dbb':10200,
    'sbb':10300,
    'cbb':11300,
    'bbb':14400,

}

# ── FIT PARAMETERS ────────────────────────────────────────────────
# Curvature cancellation — baryon (tetrahedral)
m1s  = (PDG['uds!'] - m11)        / 2      # 401.6 MeV  1st×s singlet
mss  = PDG['uss']   - 2*m1s                # 511.7 MeV  s×s
m1c  = (PDG['udc!'] - m11) / 2             # 987.0 MeV  1st×c singlet
msc  = PDG['usc!']  - m1s  - m1c           # 1079.4 MeV s×c
mcc  = PDG['dcc']   - 2*m1c                # 1646.1 MeV c×c
m1b  = (PDG['udb!'] - m11) / 2             # 2653.5 MeV 1st×b singlet
msb  = PDG['usb!']  - m1s  - m1b           # 2736.8 MeV s×b
mcb  = PDG['ucb!']  - m1c  - m1b           # 3365.3 MeV c×b

# Curvature cancellation — vector (tetrahedral)
# Vector meson = 2×baryon_pair + m1 + ms/mc/mb (gluon-offset terminal loop)
# Exception: heavy pairs use half of pseudoscalar energy
mss_v  = PDG['ss_bar%']  / 2               # 509.7 MeV
mcc_v  = PDG['cc_bar%']  / 2               # 1548.5 MeV
mbb_v  = PDG['bb_bar%']  / 2               # 4730.2 MeV
m1 = (PDG['ud_bar%'] - 2*m11)/2
ms = PDG['us_bar%'] - 2*m1s - m1
mc = PDG['cu_bar%'] - 2*m1c - m1
mb = PDG['ub_bar%'] - 2*m1b - m1
mbb  = (PDG['bb_bar%'] - 2*mb)             / 2     # 4730.2 MeV b×b (from Υ/2)

# Curvature cancellation — pseudoscalar (planar)
m1s0 = PDG['us_bar'] - m10              # 424.2 MeV
mss0 = (600.0 - 2.8)                   # ~298.6 MeV (f0(600)/σ meson)
m1c0 = PDG['cu_bar'] - m10              # 1795.3 MeV
msc0 = PDG['cs_bar']                     # 1968.3 MeV (full Ds+)
mcc0 = PDG['cc_bar']                     # 2983.9 MeV (ηc)
m1b0 = PDG['ub_bar'] - m10              # 5209.8 MeV
msb0 = PDG['sb_bar']                     # 5366.9 MeV
mcb0 = PDG['cb_bar']                     # 6274.5 MeV
mbb0 = PDG['bb_bar']                     # 9859.4 MeV

# Twist contribution
# The singlet (!) is the MINIMUM twist configuration
mfds  = PDG['uds']  - PDG['uds!']          #  76.9 MeV  d↔s  twsit
mfcu  = PDG['udc']  - PDG['udc!']          # 166.4 MeV  u↔c
mfdb  = PDG['udb']  - PDG['udb!']          # 193.8 MeV  u/d↔b
mfsb  = PDG['usb']  - PDG['usb!']          # 143.1 MeV  s↔b
mfcb  = PDG['ucb']  - PDG['ucb!']          #  31.5 MeV  c↔b
mfdss = PDG['dss']  - PDG['uss']           #   6.8 MeV  d↔ss (isospin split Ξ)
mf1sc = PDG['usc']  - PDG['usc!']          #   6.8 MeV  d↔ss (isospin split Ξ)

# Excitation — J=3/2 flip energy (one quark to mirror face)
# Decreases sharply with quark generation (heavier quark → less mobile)
mes   = PDG['uds*'] - PDG['uds']           # 191.1 MeV  s-flip
mec   = PDG['udc*'] - PDG['udc']           #  64.6 MeV  c-flip
meb   = PDG['udb*'] - PDG['udb']           #  19.6 MeV  b-flip
# Multi-strange environments reduce the effective excitation:
mess  = PDG['uss*'] - PDG['uss']           # 216.9 MeV  flip in Ξ (2s base)
messs  = PDG['sss*'] - 3*mss               # 137.4 MeV  flip in Ω (3s base)

# ── UNIFIED MODEL MAP ─────────────────────────────────────────────
# Each entry: (name, tag, calc_expr) — evaluated lazily at runtime
# Tags: ! singlet, % vector, * J=3/2, ^ prime, _bar antiquark meson

def _C(tag, expr):
    """Build a model entry: (tag, calculated, pdg_or_None)."""
    val = expr
    ref = PDG.get(tag)
    return (tag, val, ref)

# Singlet mass: (1st,1st) pair uses tilted geometry
def _sing(tilt_val, pair1, pair2):
    """m_singlet = tilt_11 + pair1 + pair2"""
    return tilt_val + pair1 + pair2

# ── BUILD THE UNIFIED TABLE ────────────────────────────────────────
MODEL = [
  # (display_name, tag, calc, comment)

  # ── PSEUDOSCALAR MESONS ──────────────────────────────────────────
  ("π±   ud",       'ud_bar',    2*m10,                 ""),
  ("π⁰   dd",       'dd_bar',    2*m10,                 ""),
  ("K±   us",       'us_bar',    m1s0 + m10,            "cal"),
  ("K0   ds",       'ds_bar',    m1s0 + m10,            ""),
  ("D0   cu",       'cu_bar',    m1c0 + m10,            "cal"),
  ("D+   cd",       'cd_bar',    m1c0 + m10,            ""),
  ("Ds+  cs",       'cs_bar',    msc0,                  "cal"),
  ("ηc   cc",       'cc_bar',    mcc0,                  "cal"),
  ("B+   ub",       'ub_bar',    m1b0 + m10,            "cal"),
  ("B0   db",       'db_bar',    m1b0 + m10,            ""),
  ("Bs   sb",       'sb_bar',    msb0,                  "cal"),
  ("Bc+  cb",       'cb_bar',    mcb0,                  "cal"),
  ("χb0  bb",       'bb_bar',    mbb0,                  "cal"),

  # ── VECTOR MESONS ────────────────────────────────────────────────
  ("ρ/ω  ud",       'ud_bar%',   2*m11 + 2*m1,           "cal"),
  ("K+*  us",       'us_bar%',   2*m1s + m1 + ms,        "cal"),
  ("K0*  ds",       'ds_bar%',   2*m1s + m1 + ms,        ""),
  ("φ    ss",       'ss_bar%',   2*mss_v,                "cal"),
  ("D0*  cu",       'cu_bar%',   2*m1c + m1 + mc,        "cal"),
  ("D+*  cd",       'cd_bar%',   2*m1c + m1 + mc,        ""),
  ("Ds*  cs",       'cs_bar%',   2*msc + mc + mc/2,      ""),
  ("J/ψ  cc",       'cc_bar%',   2*mcc_v,                "cal"),
  ("B*+  ub",       'ub_bar%',   2*m1b + m1 + mb,        "cal"),
  ("B0+  ub",       'db_bar%',   2*m1b + m1 + mb,        ""),
  ("Υ    bb",       'bb_bar%',   2*mbb_v,                "cal"),

  # ── 1ST GEN BARYONS ──────────────────────────────────────────────
  ("p    uud",      'uud',       3*m11,                  ""),
  ("n    udd",      'udd',       3*m11,                  ""),
  ("Δ    uuu*",     'uuu*',      m11 + 2*(m11+m11r)/2,   "geom avg"),

  # ── STRANGE BARYONS J=1/2 ────────────────────────────────────────
  # Singlet (!)
  ("Λ    uds!",     'uds!',      m11 + 2*m1s,            "cal"),
  # Triplet: full m11 + two 1st×s + twist mfds
  ("Σ0   uds",      'uds',       m11 + 2*m1s + mfds,     "cal"),
  ("Σ+   uus",      'uus',       m11 + 2*m1s + mfds,     ""),
  ("Σ-   dds",      'dds',       m11 + 2*m1s + mfds,     ""),
  # Ξ: two s-arcs + one 1st×s; d precedes gives fdss twist
  ("Ξ0   uss",      'uss',       2*m1s + mss,            "cal"),
  ("Ξ-   dss",      'dss',       2*m1s + mss + mfdss,    "cal"),

  # ── STRANGE J=3/2 ────────────────────────────────────────────────
  # Excitation = + mes (one s flips) applied to J=1/2 triplet base
  ("Σ*0  uds*",     'uds*',      m11 + 2*m1s + mfds + mes,  "cal"),
  ("Σ*+  uus*",     'uus*',      m11 + 2*m1s + mfds + mes,  ""),
  ("Σ*-  dds*",     'dds*',      m11 + 2*m1s + mfds + mes,  ""),
  ("Ξ*0  uss*",     'uss*',      2*m1s + mss + mess,        "cal"),
  ("Ξ*-  dss*",     'dss*',      2*m1s + mss + mfdss + mess,""),
  ("Ω-   sss*",     'sss*',      3*mss + messs,              "cal"),

  # ── CHARM BARYONS J=1/2 ──────────────────────────────────────────
  # Singlet:
  ("Λc+  udc!",     'udc!',      m11 + 2*m1c,                "cal"),
  # Triplet: full m11 + two 1st×c + twist mfcu
  ("Σc+  udc",      'udc',       m11 + 2*m1c + mfcu,         "cal"),
  ("Σc++ uuc",      'uuc',       m11 + 2*m1c + mfcu,         ""),
  ("Σc0  ddc",      'ddc',       m11 + 2*m1c + mfcu,         ""),
  # Ξc singlet: s×c + 1st×s + 1st×c
  ("Ξc+  usc!",     'usc!',      m1s + m1c + msc,            "cal"),
  ("Ξc0  dsc!",     'dsc!',      m1s + m1c + msc,            ""),
  # Ξ'c prime: singlet + twist (u before c)
  ("Ξ'c+ usc",      'usc',       m1s + m1c + msc + mf1sc,     "cal"),
  ("Ξ'c0 dsc",      'dsc',       m1s + m1c + msc + mf1sc,     ""),
  # Ωc: two s×c + one s×s
  ("Ωc0  ssc",      'ssc',       2*msc + mss,                ""),
  # Ξcc: two 1st×c + c×c
  ("Ξcc+ dcc",      'dcc',       2*m1c + mcc,                "cal"),
  ("Ξcc++ ucc",     'ucc',       2*m1c + mcc,                ""),
  ("Ωcc+ scc",      'scc',       2*msc + mcc,                ""),

  # ── CHARM J=3/2 ──────────────────────────────────────────────────
  ("Σ*c+ udc*",     'udc*',      m11 + 2*m1c + mfcu + mec,  "cal"),
  ("Σ*c++ uuc*",    'uuc*',      m11 + 2*m1c + mfcu + mec,  ""),
  ("Σ*c0 ddc*",     'ddc*',      m11 + 2*m1c + mfcu + mec,  ""),
  ("Ξ*c+ usc*",     'usc*',      m1s + m1c + msc + mf1sc + mec, ""),
  ("Ξ*c0 dsc*",     'dsc*',      m1s + m1c + msc + mf1sc + mec, ""),
  ("Ω*c0 ssc*",     'ssc*',      2*msc + mss + mec,          ""),
  ("Ξcc*++ ucc*",   'ucc*',      2*m1c + mcc + mec,          ""),
  ("Ξcc*+ dcc*",    'dcc*',      2*m1c + mcc + mec,          ""),

  # ── BOTTOM BARYONS J=1/2 ─────────────────────────────────────────
  # Singlet:
  ("Λb0  udb!",     'udb!',      m11 + 2*m1b,                "cal"),
  # Triplet: full m11 + two 1st×b + twist mfdb
  ("Σb0  udb",      'udb',       m11 + 2*m1b + mfdb,         "cal"),
  ("Σb+  uub",      'uub',       m11 + 2*m1b + mfdb,         ""),
  ("Σb-  ddb",      'ddb',       m11 + 2*m1b + mfdb,         ""),
  # Ξb singlet: s×b + 1st×s + 1st×b
  ("Ξb0  usb!",     'usb!',      m1s + m1b + msb,            "cal"),
  ("Ξb-  dsb!",     'dsb!',      m1s + m1b + msb,            ""),
  # Ξ'b prime: singlet + twist
  ("Ξ'b0 usb",      'usb',       m1s + m1b + msb + mfsb,     "cal"),
  ("Ξ'b- dsb",      'dsb',       m1s + m1b + msb + mfsb,     ""),
  # Ξbc: 1st×b + 1st×c + c×b
  ("Ξbc0 ucb!",     'ucb!',      m1c + m1b + mcb,            "cal"),
  ("Ξ'bc ucb",      'ucb',       m1c + m1b + mcb + mfcb,     "cal"),
  # Ωb: two s×b + one s×s
  ("Ωb-  ssb",      'ssb',       2*msb + mss + mfsb,            ""),

  # ── BOTTOM J=3/2 ─────────────────────────────────────────────────
  ("Σ*b0 udb*",     'udb*',      m11 + 2*m1b + mfdb + meb,  "cal"),
  ("Σ*b+ uub*",     'uub*',      m11 + 2*m1b + mfdb + meb,  ""),
  ("Σ*b- ddb*",     'ddb*',      m11 + 2*m1b + mfdb + meb,  ""),

  # ── UNMEASURED PREDICTIONS ───────────────────────────────────────
  ("Ωcc*+ scc*",    'scc*',       2*msc + mcc + mec,          "pred"),
  ("Ωbc  scb",      'scb',        msb + mcb + msc,            "pred"),
  ("Ξbb- ubb",      'ubb',        2*m1b + mbb,                "pred"),
  ("Ξbb0 dbb",      'dbb',        2*m1b + mbb,                "pred"),
  ("Ωbb- sbb",      'sbb',        2*msb + mbb,                "pred"),
  ("Ωbbc cbb",      'cbb',        2*mcb + mbb,                "pred"),
  ("Ωbbb bbb",      'bbb',        3*mbb,                      "pred"),
]

# ── OUTPUT ────────────────────────────────────────────────────────
print("=" * 82)
print("  PARTICLE MASSES FROM THE QUANTUM OF ACTION")
print("=" * 82)
print(f"""
  Derived from electron (no free parameters):
    me = {me:5.3f} MeV    m10 = {m1:5.3f} MeV    m11 = {m11:5.3f} MeV
    mu = {mu:5.3f} MeV    m11r = {m11r:4.1f} MeV   (resonance flip)

  Curvature cancellation — baryon (tetrahedral):
    m11 = {m11:6.1f}   m1s = {m1s:6.1f}   m1c = {m1c:6.1f}   m1b = {m1b:6.1f}
    mss = {mss:6.1f}   msc = {msc:6.1f}   msb = {msb:6.1f}
    mcc = {mcc:6.1f}   mcb = {mcb:6.1f}
    mbb = {mbb:6.1f}

  Central charm
    mc m1c-m1s = {m1c-m1s:.1f}

  Curvature cancellation — pseudoscalar meson (planar):
    m1s0 = {m1s0:6.1f}   m1c0 = {m1c0:6.1f}   m1b0 = {m1b0:6.1f}
    mss0 = {mss0:6.1f}   mcc0 = {mcc0:6.1f}   msc0 = {msc0:6.1f}   msb0 = {msb0:6.1f}

  Curvature cancellation with antiquark vs quark — vector meson (tetrahedron):
    mss_v  = {mss_v:6.1f}   mcc_v  = {mcc_v:6.1f}   mbb_v  = {mbb_v:6.1f}
    ms  = {ms:6.1f}   mc  = {mc:6.1f}   mb  = {mb:6.1f}

  Twist contribution — baryon (tetrahedral):
    mfds = {mfds:.1f}   mfcu = {mfcu:.1f}   mf1sc = {mf1sc:.1f}   mfdb = {mfdb:.1f}   mfsb = {mfsb:.1f}   mfcb = {mfcb:.1f}   mfdss = {mfdss:.1f}

  Excitation (J=3/2 flip, decreases with quark generation):
    mes = {mes:.1f}   mec = {mec:.1f}   meb = {meb:.1f}
    mess = {mess:.1f} (Ξ* context)   messs = {messs:.1f} (Ω context)
""")

HDR = f"  {'Name':<14} {'Tag':<12} {'Calc':>8}  {'PDG':>8}  {'Diff':>8}  {'%':>6}  Note"
SEP = "  " + "─" * 74
PREDICTION_TAGS = {'scb','ubb','dbb','sbb','cbb','bbb','scc*'}

sections = [
    ("PSEUDOSCALAR MESONS", lambda t: t not in PREDICTION_TAGS and t is not None and '_bar' in t and '%' not in t),
    ("VECTOR MESONS", lambda t: t not in PREDICTION_TAGS and t is not None and '%' in t),
    ("1ST GEN BARYONS", lambda t: t not in PREDICTION_TAGS and t is not None and all(q in 'ud*' for q in t.replace('*',''))),
    ("STRANGE BARYONS J=1/2", lambda t: t not in PREDICTION_TAGS and t is not None and 's' in t and '*' not in t and 'c' not in t and 'b' not in t and '_bar' not in t),
    ("STRANGE BARYONS J=3/2", lambda t: t not in PREDICTION_TAGS and t is not None and 's' in t and '*' in t and 'c' not in t and 'b' not in t and '_bar' not in t),
    ("CHARM BARYONS J=1/2", lambda t: t not in PREDICTION_TAGS and t is not None and 'c' in t and '*' not in t and 'b' not in t and '_bar' not in t),
    ("CHARM BARYONS J=3/2", lambda t: t not in PREDICTION_TAGS and t is not None and 'c' in t and '*' in t and 'b' not in t and '_bar' not in t),
    ("BOTTOM BARYONS J=1/2", lambda t: t not in PREDICTION_TAGS and t is not None and 'b' in t and '*' not in t and '_bar' not in t),
    ("BOTTOM BARYONS J=3/2", lambda t: t not in PREDICTION_TAGS and t is not None and 'b' in t and '*' in t and '_bar' not in t),
    ("PREDICTIONS", lambda t: t in PREDICTION_TAGS),
]

printed = set()
for section_name, pred in sections:
    rows = [(n,tg,c,note) for n,tg,c,note in MODEL
            if pred(tg) and tg not in printed]
    if not rows: continue
    print(f"\n{'─'*82}\n  {section_name}\n{'─'*82}")
    print(HDR); print(SEP)
    for name, tag, calc, note in rows:
        if tag and tag not in PREDICTION_TAGS:
            printed.add(tag)
        #if tag: printed.add(tag)
        ref = PDG.get(tag) if tag else None
        diff = calc - ref if ref else None
        pct  = 100*abs(diff)/ref if ref else None
        sym = ("cal" if abs(diff)<0.01 else "✓" if pct<2 else "~" if pct<6 else "✗") if pct is not None else "pred"
        tag_s = tag if tag else "—"
        if ref:
            print(f"  {name:<14} {tag_s:<12} {calc:8.1f}  {ref:8.1f}  {diff:+8.1f}  {pct:5.1f}%  {sym}  {note}")
        else:
            print(f"  {name:<14} {tag_s:<12} {calc:8.1f}  {'—':>8}  {'—':>8}  {'—':>6}  {sym}  {note}")


  PARTICLE MASSES FROM THE QUANTUM OF ACTION

  Derived from electron (no free parameters):
    me = 0.511 MeV    m10 = 75.117 MeV    m11 = 312.513 MeV
    mu = 0.170 MeV    m11r = 601.6 MeV   (resonance flip)

  Curvature cancellation — baryon (tetrahedral):
    m11 =  312.5   m1s =  401.6   m1c =  987.0   m1b = 2653.5
    mss =  511.7   msc = 1079.3   msb = 2736.8
    mcc = 1646.0   mcb = 3365.2
    mbb = 4787.7

  Central charm
    mc m1c-m1s = 585.4

  Curvature cancellation — pseudoscalar meson (planar):
    m1s0 =  424.2   m1c0 = 1795.3   m1b0 = 5209.8
    mss0 =  597.2   mcc0 = 2983.9   msc0 = 1968.3   msb0 = 5366.9

  Curvature cancellation with antiquark vs quark — vector meson (tetrahedron):
    mss_v  =  509.7   mcc_v  = 1548.5   mbb_v  = 4730.1
    ms  =   13.4   mc  =  -42.1   mb  =  -57.5

  Twist contribution — baryon (tetrahedral):
    mfds = 76.9   mfcu = 166.4   mf1sc = 110.3   mfdb = 193.8   mfsb = 143.1   mfcb = 31.5   mfdss = 6.8

  Excitation (J=3/2 flip, decrease

In [16]:
#@title STRING SOURCE THEORY
"""
PARTICLE MASSES FROM THE QUANTUM OF ACTION
===========================================
Annila, E., & Annila, A. (2026). Particles and Vacuum as Strings from the
Quantum of Action, Zenodo. https://doi.org/10.5281/zenodo.18669551

This code exemplifies how to treat particles as sources of surrounding fields,
to calculate cross section and decay rate of an electron using Schwinger's
source theory.

    inputs :  m (mass = strength of the density source J_rho)
              alpha = e^2/4pi (charge = strength of the winding/current source J^mu)
    outputs:  (1) Compton / Thomson scattering   e- + gamma -> e- + gamma
              (2) annihilation                   e- + e+    -> gamma + gamma
              (3) para-positronium decay rate    p-Ps       -> gamma + gamma

Chain of logic as in the Appendix A
----------------------------------------
    S_vac --> D_+ --> W[J] = 1/2 int J D_+ J --> M --> (sigma, Gamma)

  * Sources. The electron string generates the conserved current
    J^mu(p',p) = e * ubar(p') gamma^mu u(p), i.e., Dirac current of closed
    chiral string in the Zitterbewegung picture. The electong mass m enters
    through the propagation of the same source between emission and absorption.
  * Vacuum response. Exchange of a vacuum (phase) disturbance between two
    conserved vector sources is  W12 = - int J1^mu D_+ J2_mu  with the massless
    propagator  D_+^{mu nu}(k) = -g^{mu nu}/k^2  (Feynman gauge). Its static
    limit is the Coulomb potential  U(r) = q1 q2/(4 pi r), i.e. -alpha/r for e+e-.
  * Source propagation. Between two photon emissions/absorptions the electron
    source propagates with  i(p-slash + m)/(p^2 - m^2)  (same input m).
  * Observables from M: Gamma = (1/2M) int |M|^2 dPhi_n ,
                        dsigma = |M|^2 dPhi_2 / (4 sqrt((p1.p2)^2 - m1^2 m2^2)).

At tree level, the source theory and Feynman-diagram QFT give identical,standard
amplitudes below (Schwinger 1970; Milton 2015); what the string picture supplies
is the sources (m, e, spin-1/2 circulation). Everything is evaluated numerically
from explicit Dirac spinors, whereas closed formulas (Klein-Nishina, Dirac)
serve only as independent checks.

Units: hbar = c = 1 internally (MeV); results converted to SI at the end.
"""
import numpy as np

# ----------------------------------------------------------------------------
# Input parameters (CODATA 2022)
# ----------------------------------------------------------------------------
ALPHA = 7.2973525643e-3          # fine-structure constant  (= e^2/4pi, = e^2 Z_0/2h)
M_E = 0.51099895069              # electron mass  m c^2  [MeV]
HBAR_MEV_S = 6.582119569e-22     # hbar [MeV s]
HBARC_MEV_FM = 197.3269804       # hbar c [MeV fm]
E2 = 4.0 * np.pi * ALPHA         # e^2 in Heaviside-Lorentz natural units

# ----------------------------------------------------------------------------
# Dirac algebra, metric (+,-,-,-)
# ----------------------------------------------------------------------------
I2 = np.eye(2, dtype=complex)
Z2 = np.zeros((2, 2), dtype=complex)
SIG = [np.array([[0, 1], [1, 0]], dtype=complex),
       np.array([[0, -1j], [1j, 0]], dtype=complex),
       np.array([[1, 0], [0, -1]], dtype=complex)]
G0 = np.block([[I2, Z2], [Z2, -I2]])
GI = [np.block([[Z2, s], [-s, Z2]]) for s in SIG]
ID4 = np.eye(4, dtype=complex)


def dot(a, b):
    """Minkowski product of four-vectors a=(a0,ax,ay,az)."""
    return a[0] * b[0] - a[1] * b[1] - a[2] * b[2] - a[3] * b[3]


def slash(a):
    """a-slash = gamma^mu a_mu."""
    return a[0] * G0 - a[1] * GI[0] - a[2] * GI[1] - a[3] * GI[2]


def sigma_dot(p3):
    return p3[0] * SIG[0] + p3[1] * SIG[1] + p3[2] * SIG[2]


def u_spinor(p3, s, m=M_E):
    """Electron source spinor, normalised ubar u = 2m."""
    E = np.sqrt(m * m + np.dot(p3, p3))
    chi = np.array([1, 0], dtype=complex) if s == 0 else np.array([0, 1], dtype=complex)
    return np.concatenate([np.sqrt(E + m) * chi, sigma_dot(p3) @ chi / np.sqrt(E + m)])


def v_spinor(p3, s, m=M_E):
    """Positron (oppositely wound string) spinor, vbar v = -2m."""
    E = np.sqrt(m * m + np.dot(p3, p3))
    eta = np.array([1, 0], dtype=complex) if s == 0 else np.array([0, 1], dtype=complex)
    return np.concatenate([sigma_dot(p3) @ eta / np.sqrt(E + m), np.sqrt(E + m) * eta])


def bar(psi):
    return psi.conj() @ G0


def four(E, p3):
    return np.array([E, p3[0], p3[1], p3[2]], dtype=float)


def pol_vectors(n):
    """Two real transverse polarisation four-vectors for photon direction n."""
    n = np.asarray(n, dtype=float) / np.linalg.norm(n)
    a = np.array([1.0, 0, 0]) if abs(n[0]) < 0.9 else np.array([0, 1.0, 0])
    e1 = np.cross(n, a); e1 /= np.linalg.norm(e1)
    e2 = np.cross(n, e1)
    return [np.array([0.0, *e1]), np.array([0.0, *e2])]


# ----------------------------------------------------------------------------
# Vacuum exchange between two sources: static limit of W12
# ----------------------------------------------------------------------------
def exchange_potential(r, q1_over_e, q2_over_e):
    """U(r) = q1 q2/(4 pi r) from W12 = -int J1^mu D_+ J2_mu (static, m_gamma=0).
    Like charges repel, e+ e- attract: U = -alpha/r for the pair."""
    return q1_over_e * q2_over_e * ALPHA / r          # in units hbar = c = 1


def psi0_squared_positronium(m=M_E):
    """|psi(0)|^2 of the 1S state of two sources (m, +-e) bound by U = -alpha/r:
    reduced mass m/2, Bohr radius a = 2/(m alpha), |psi(0)|^2 = 1/(pi a^3)."""
    a = 2.0 / (m * ALPHA)
    return 1.0 / (np.pi * a ** 3)


# ----------------------------------------------------------------------------
# Tree amplitudes built from the source current and the source propagator
# ----------------------------------------------------------------------------
def amp_compton(p, s, k, eps, pp, sp, kp, epsp, m=M_E):
    """e-(p,s) + gamma(k,eps) -> e-(p',s') + gamma(k',eps').   (e^2 factored in)"""
    ub = bar(u_spinor(pp[1:], sp, m))
    u = u_spinor(p[1:], s, m)
    ks, kps = slash(k), slash(kp)
    d1 = dot(p + k, p + k) - m * m
    d2 = dot(p - kp, p - kp) - m * m
    A = (slash(epsp) @ (slash(p) + ks + m * ID4) @ slash(eps)) / d1 \
        + (slash(eps) @ (slash(p) - kps + m * ID4) @ slash(epsp)) / d2
    return E2 * (ub @ A @ u)


def amp_annihilation(p1, s1, p2, s2, k1, e1, k2, e2, m=M_E):
    """e-(p1,s1) + e+(p2,s2) -> gamma(k1,e1) + gamma(k2,e2).   (e^2 factored in)"""
    vb = bar(v_spinor(p2[1:], s2, m))
    u = u_spinor(p1[1:], s1, m)
    d1 = dot(p1 - k1, p1 - k1) - m * m
    d2 = dot(p1 - k2, p1 - k2) - m * m
    A = (slash(e2) @ (slash(p1) - slash(k1) + m * ID4) @ slash(e1)) / d1 \
        + (slash(e1) @ (slash(p1) - slash(k2) + m * ID4) @ slash(e2)) / d2
    return E2 * (vb @ A @ u)


# ----------------------------------------------------------------------------
# (1) Scattering: Compton cross section, Klein-Nishina and Thomson limit
# ----------------------------------------------------------------------------
def compton_dsigma_domega(omega, cos_t, m=M_E):
    """Lab-frame dsigma/dOmega [1/MeV^2] for electron initially at rest."""
    sin_t = np.sqrt(1 - cos_t ** 2)
    omp = omega / (1 + (omega / m) * (1 - cos_t))
    p = four(m, [0, 0, 0])
    k = four(omega, [0, 0, omega])
    kp = four(omp, [omp * sin_t, 0, omp * cos_t])
    pp = p + k - kp
    pols_in = pol_vectors([0, 0, 1])
    pols_out = pol_vectors([sin_t, 0, cos_t])
    tot = 0.0
    for s in (0, 1):
        for sp in (0, 1):
            for e in pols_in:
                for ep in pols_out:
                    tot += abs(amp_compton(p, s, k, e, pp, sp, kp, ep, m)) ** 2
    avg = tot / 4.0                       # average initial e spin and photon pol.
    return avg * (omp / omega) ** 2 / (64 * np.pi ** 2 * m ** 2)


def klein_nishina_dsigma_domega(omega, cos_t, m=M_E):
    """Closed-form check (not used in the calculation)."""
    omp = omega / (1 + (omega / m) * (1 - cos_t))
    r = omp / omega
    return ALPHA ** 2 / (2 * m ** 2) * r ** 2 * (r + 1 / r - (1 - cos_t ** 2))


def total_compton(omega, n=48, m=M_E):
    x, w = np.polynomial.legendre.leggauss(n)
    f = np.array([compton_dsigma_domega(omega, c, m) for c in x])
    return 2 * np.pi * np.sum(w * f)


# ----------------------------------------------------------------------------
# (2) Annihilation cross section and (3) para-positronium decay
# ----------------------------------------------------------------------------
def annihilation_spin_pol_sums(P, cos_t, m=M_E):
    """CM frame, electron momentum +P z-hat.  Returns (sum|M|^2 over everything,
    A-matrix summed pol. structure) for photon direction at angle theta."""
    E = np.sqrt(m * m + P * P)
    sin_t = np.sqrt(1 - cos_t ** 2)
    n = np.array([sin_t, 0, cos_t])
    p1 = four(E, [0, 0, P]); p2 = four(E, [0, 0, -P])
    k1 = four(E, E * n); k2 = four(E, -E * n)
    pols1, pols2 = pol_vectors(n), pol_vectors(-n)
    tot = 0.0
    A = np.zeros((2, 2), dtype=complex)         # spin matrix A[s1, s2], pol-summed power
    singlet = 0.0; triplet = 0.0
    for e1 in pols1:
        for e2 in pols2:
            Ms = np.array([[amp_annihilation(p1, s1, p2, s2, k1, e1, k2, e2, m)
                            for s2 in (0, 1)] for s1 in (0, 1)])
            tot += np.sum(np.abs(Ms) ** 2)
            # decomposition A = a*1 + b.sigma  (singlet = trace part)
            a = np.trace(Ms) / 2.0
            singlet += 2 * abs(a) ** 2
            triplet += np.sum(np.abs(Ms) ** 2) - 2 * abs(a) ** 2
    return tot, singlet, triplet


def annihilation_sigma_v(P, n=32, m=M_E):
    """Spin-averaged sigma * v_rel for e- e+ -> 2 gamma, and singlet / triplet parts."""
    E = np.sqrt(m * m + P * P)
    x, w = np.polynomial.legendre.leggauss(n)
    tot = sing = trip = 0.0
    for c, wi in zip(x, w):
        t, s_, r_ = annihilation_spin_pol_sums(P, c, m)
        tot += wi * t; sing += wi * s_; trip += wi * r_
    # sigma v_rel = 1/(4 E^2) * (1/2 identical photons) * int dPhi2 |M|^2,  dPhi2 = dOmega/(32 pi^2)
    fac = (1.0 / (4 * E * E)) * 0.5 * (2 * np.pi) / (32 * np.pi ** 2)
    return fac * tot / 4.0, fac * sing, fac * trip     # avg over 4 spin states; singlet, triplet = |state|^2-sums


def annihilation_sigma(P, m=M_E):
    E = np.sqrt(m * m + P * P)
    v_rel = 2 * P / E
    return annihilation_sigma_v(P, m=m)[0] / v_rel


def dirac_annihilation_sigma(gamma_lab, m=M_E):
    """Dirac's closed formula (check only); gamma_lab = positron gamma in e- rest frame."""
    re = ALPHA / m
    g = gamma_lab
    b = np.sqrt(g * g - 1)
    return np.pi * re ** 2 / (g + 1) * ((g * g + 4 * g + 1) / (g * g - 1) * np.log(g + b) - (g + 3) / b)


def parapositronium_rate(m=M_E):
    """Gamma(p-Ps -> 2 gamma) = |psi(0)|^2 * (sigma v)_singlet  [MeV]."""
    P = 1e-4 * m                                   # threshold limit
    _, sing, trip = annihilation_sigma_v(P, m=m)
    # 'sing' is sum over |tr A|^2/2-type states: singlet cross section = sing/1 (state-normalised);
    # equivalently 4 x spin average, because the triplet cannot go to 2 gamma (C-parity).
    sigv_singlet = sing
    return psi0_squared_positronium(m) * sigv_singlet, sing, trip, annihilation_sigma_v(P, m=m)[0]


# ----------------------------------------------------------------------------
if __name__ == "__main__":
    fm2_to_m2 = 1e-30
    conv = HBARC_MEV_FM ** 2 * fm2_to_m2           # MeV^-2 -> m^2
    print("Inputs: alpha = %.10e   m_e c^2 = %.8f MeV\n" % (ALPHA, M_E))

    # ---- (1) scattering --------------------------------------------------
    print("(1) Compton scattering from the electron source (m, e)")
    for om in (0.1, 0.511, 1.0):
        c = 0.3
        print("    omega=%5.3f MeV, cos=0.3: dsigma/dOmega  amplitude: %.6e  Klein-Nishina: %.6e  [MeV^-2]"
              % (om, compton_dsigma_domega(om, c), klein_nishina_dsigma_domega(om, c)))
    om_th = 1e-6                                   # 1 eV photon: Thomson limit
    sig_T = total_compton(om_th) * conv
    sig_T_ana = 8 * np.pi / 3 * (ALPHA / M_E) ** 2 * conv
    sig_T_ref = 6.6524587e-29                      # CODATA electron Thomson cross section [m^2]
    print("    Thomson limit (omega -> 0):  sigma = %.7e m^2  (= %.5f barn)" % (sig_T, sig_T * 1e28))
    print("      8pi/3 (alpha/m)^2        = %.7e m^2" % sig_T_ana)
    print("      CODATA reference value   = %.7e m^2   ratio = %.7f" % (sig_T_ref, sig_T / sig_T_ref))
    print("    (CODATA's value is itself computed from alpha and m_e: a test of the calculation,")
    print("     not an independent measurement.)\n")

    # ---- (2) annihilation ---------------------------------------------------
    print("(2) Annihilation e- e+ -> 2 gamma from the same sources (crossing)")
    for P in (0.3 * M_E, 1.0 * M_E, 3.0 * M_E):
        E = np.hypot(M_E, P)
        g_lab = 2 * (E / M_E) ** 2 - 1
        s_num = annihilation_sigma(P) * conv
        s_dir = dirac_annihilation_sigma(g_lab) * conv
        print("    P_cm=%.3f m_e:  sigma = %.6e m^2   Dirac formula = %.6e m^2   ratio %.8f"
              % (P / M_E, s_num, s_dir, s_num / s_dir))
    print()

    # ---- (3) para-positronium decay -----------------------------------------
    print("(3) Para-positronium -> 2 gamma:  Gamma = |psi(0)|^2 (sigma v)_singlet")
    G, sing, trip, avg = parapositronium_rate()
    G_s = G / HBAR_MEV_S                           # 1/s
    sv_exact = np.pi * ALPHA ** 2 / M_E ** 2
    print("    Coulomb potential from source exchange: U(r) = -alpha/r  -> |psi(0)|^2 = (m alpha)^3/(8 pi) = %.6e MeV^3"
          % psi0_squared_positronium())
    print("    spin-averaged sigma*v at threshold = %.6e MeV^-2   (pi alpha^2/m^2 = %.6e)" % (avg, sv_exact))
    print("    triplet part of the 2-gamma amplitude / singlet part = %.2e   (C-parity: zero)" % (trip / sing))
    print("    4 x spin-averaged = %.6e,  singlet = %.6e   (equal)" % (4 * avg, sing))
    print("    Gamma(p-Ps) tree level      = %.4f  1/us  = %.5f 1/ns  (tau = %.2f ps)"
          % (G_s * 1e-6, G_s * 1e-9, 1e12 / G_s))
    print("    closed form alpha^5 m/2     = %.4f  1/us" % (0.5 * ALPHA ** 5 * M_E / HBAR_MEV_S * 1e-6))
    one_loop = G_s * (1 - ALPHA / np.pi * (5 - np.pi ** 2 / 4))
    print("    measured (Al-Ramadhan & Gidley 1994) = 7990.9 +- 1.7  1/us")
    print("    tree level vs measured: %+.2f %%" % (100 * (G_s * 1e-6 / 7990.9 - 1)))
    print("    for orientation only, the known O(alpha) radiative correction (Harris & Brown 1957),")
    print("    not computed here, gives %.2f 1/us, %+.2f %% from the measurement" %
          (one_loop * 1e-6, 100 * (one_loop * 1e-6 / 7990.9 - 1)))

Inputs: alpha = 7.2973525643e-03   m_e c^2 = 0.51099895 MeV

(1) Compton scattering from the electron source (m, e)
    omega=0.100 MeV, cos=0.3: dsigma/dOmega  amplitude: 8.727767e-05  Klein-Nishina: 8.727767e-05  [MeV^-2]
    omega=0.511 MeV, cos=0.3: dsigma/dOmega  amplitude: 4.862792e-05  Klein-Nishina: 4.862792e-05  [MeV^-2]
    omega=1.000 MeV, cos=0.3: dsigma/dOmega  amplitude: 3.416596e-05  Klein-Nishina: 3.416596e-05  [MeV^-2]
    Thomson limit (omega -> 0):  sigma = 6.6524327e-29 m^2  (= 0.66524 barn)
      8pi/3 (alpha/m)^2        = 6.6524587e-29 m^2
      CODATA reference value   = 6.6524587e-29 m^2   ratio = 0.9999961
    (CODATA's value is itself computed from alpha and m_e: a test of the calculation,
     not an independent measurement.)

(2) Annihilation e- e+ -> 2 gamma from the same sources (crossing)
    P_cm=0.300 m_e:  sigma = 4.629468e-29 m^2   Dirac formula = 4.629468e-29 m^2   ratio 1.00000000
    P_cm=1.000 m_e:  sigma = 1.700265e-29 m^2   Dirac formula = 1.700

#**Particles**:

In [ ]:
#@title STANDARD MODEL STRINGS
from ipywidgets import Button, VBox, HBox, Layout, Output
from IPython.display import display, HTML
from functools import partial
import plotly.graph_objects as go

# Output widget to display the figure

class StandardModelDemo(ParticleDemo):
  def Z(particle):
    # Z combines W+ and W- to one continuous string.
    wp=Wplus()
    wm=Wminus()

    theta = -np.pi / meson_number_of_coils
    rotation_matrix = np.array([
        [np.cos(theta), -np.sin(theta), 0],
        [np.sin(theta),  np.cos(theta), 0],
        [0,              0,             1]
    ])

    pa=ParticlePosition(
        origin=np.array([0,-HelixParticle.torusRadius-ElementaryParticle.spinRadius,0]),
        normalVector=np.array([0,0,1]),
        rotationVector=rotation_matrix @ np.array([0,-1,0]),
        anchor=ParticlePosition.anchor_end,
        minorOrientation=0*np.pi,
        anchor_gluon=1
    )

    pb=ParticlePosition(
        origin=np.array([0,HelixParticle.torusRadius+ElementaryParticle.spinRadius,0]),
        normalVector=np.array([0,0,1]),
        rotationVector=rotation_matrix @ np.array([0,1,0]),
        anchor=ParticlePosition.anchor_start,
        minorOrientation=0*np.pi,
        anchor_gluon=1
    )
    if particle:
        wp.setParticlePosition(pa)
        wm.setParticlePosition(pb)
    else:
        wp.setParticlePosition(pb)
        wm.setParticlePosition(pa)
    return wp,wm
  # Buttons states for particles
  particles = {
      'u': {'particle': Up, 'antiparticle': AntiUp, 'label': "u", 'anti_label': "u̅", 'color': "red", 'anti_color': "blue"},
      'd': {'particle': Down, 'antiparticle': AntiDown, 'label': "d", 'anti_label': "d̅", 'color': "blue", 'anti_color': "red"},
      'e': {'particle': Electron, 'antiparticle': Positron, 'label': "e⁻", 'anti_label': "e⁺", 'color': "blue", 'anti_color': "red"},
      've': {'particle': Neutrino, 'antiparticle': AntiNeutrino, 'label': "νₑ", 'anti_label': "v̅ₑ", 'color': "blue", 'anti_color': "red"},
      'c': {'particle': Charm, 'antiparticle': AntiCharm, 'label': "c", 'anti_label': "u̅", 'color': "orange", 'anti_color': "purple"},
      's': {'particle': Strange, 'antiparticle': AntiStrange, 'label': "s", 'anti_label': "d̅", 'color': "purple", 'anti_color': "orange"},
      'mu': {'particle': Muon, 'antiparticle': AntiMuon, 'label': "μ⁻", 'anti_label': "μ⁺", 'color': "purple", 'anti_color': "orange"},
      'vmu': {'particle': MuonNeutrino, 'antiparticle': MuonAntiNeutrino, 'label': "νₘ", 'anti_label': "v̅ₘ", 'color': "purple", 'anti_color': "orange"},
      't': {'particle': Top, 'antiparticle': AntiTop, 'label': "t", 'anti_label': "t̅", 'color': "yellow", 'anti_color': "green"},
      'b': {'particle': Bottom, 'antiparticle': AntiBottom, 'label': "b", 'anti_label': "b̅", 'color': "green", 'anti_color': "yellow"},
      'tau': {'particle': Tau, 'antiparticle': AntiTau, 'label': "τ⁻", 'anti_label': "τ⁺", 'color': "green", 'anti_color': "yellow"},
      'vtau': {'particle': TauNeutrino, 'antiparticle': TauAntiNeutrino, 'label': "νₜ", 'anti_label': "v̅ₜ", 'color': "green", 'anti_color': "yellow"},
      'g': {'particle': Gluon, 'antiparticle': AntiGluon, 'label': "g", 'anti_label': "g̅", 'color': "lightgray", 'anti_color': "lightgray"},
      'γ': {'particle': Photon, 'antiparticle': AntiPhoton,'particle': Graviton, 'antiparticle': Graviton,'label': "γ", 'anti_label': "γ\u0305", 'G_label': "G", 'anti_G_label': "G̅", 'color': "lightgray", 'anti_color': "lightgray", 'color': "lightgray", 'anti_color': "lightgray"},
      'W': {'particle': Wminus, 'antiparticle': Wplus, 'label': "W⁻", 'anti_label': "W⁺", 'color': "blue", 'anti_color': "red"},
      'Z': {'particle': Z, 'antiparticle': Z, 'label': "Z", 'anti_label': "Z̅", 'color': "lightgray", 'anti_color': "lightgray"},
  }
  def refigure_layout(self):
    """
    Configures the layout of a Plotly figure with specific axis ranges and cube aspect ratio.
    """
    axes = HelixParticle.torusRadius + ElementaryParticle.spinRadius + 1
    axis_range = [-2*axes, 2*axes]
    # Update figure layout
    self.fig.update_layout(
        scene=dict(
            xaxis=dict(range=axis_range, visible=False),
            yaxis=dict(range=axis_range, visible=False),
            zaxis=dict(range=axis_range, visible=False),
            aspectmode="cube"  # Equal scaling for all axes
        ),
        margin=dict(l=0, r=0, t=0, b=0),
        height=400,
        width=800,
        scene_camera=dict(
            eye=dict(x=0.5, y=0.5, z=0.3)  # Closer view
        ),
        showlegend=False  # Disable legends
    )


  def __init__(self):
    self.output = Output()
    self.title = "Standard model strings"
    # Toggle function
    # Global state for 'g' button
    self.g_states = ["γ","γ̅","G","G̅"]
    self.g_colors = ["lightgray", "lightgray", "lightgray", "lightgray"]
    self.standard_model_button_states = {key: 0 if key == "γ" else 1 for key in self.particles}

    buttons = {}
    for key, data in self.particles.items():
      # Create a button for each particle
      button = Button(description=data['label'], style=dict(button_color=data['color']), layout=Layout(width="50px", height="50px", font_size="30px"))

      # Create a partial function to ensure the button gets the correct state and data, and include the event argument
      button.on_click(partial(self.on_toggle_particle,
                              button=button,
                              particle_class=data['particle'],
                              anti_particle_class=data['antiparticle'],
                              particle_key=key,
                              label=data['label'],
                              anti_label=data['anti_label'],
                              color=data['color'],
                              anti_color=data['anti_color'],
                              button_states=self.standard_model_button_states))

      buttons[key] = button

    # Organize buttons into a 4x4 grid
    button_keys = list(buttons.keys())
    button_grid = HBox([VBox([buttons[key] for key in button_keys[i:i + 4]]) for i in range(0, len(button_keys), 4)])



    self.fig = StandardModelDemo.dummy_fig()
    self.fig.show()  # Important for display
    self.refigure_layout()

    # Display the UI with the grid and output widget
    self.ui = HBox([button_grid, self.output], layout=Layout(align_items="center"))



  # Toggle function
  def on_toggle_particle(self,event, button, particle_class, anti_particle_class, particle_key, label, anti_label, color, anti_color, button_states):
    """
    Generalized toggle function for switching between a particle and its antiparticle,
    or multiple states for specific particles like 'g'.
    """
    self.clear_figure(self.output,self.fig)
    with self.output:

      if particle_key == "γ":
          # Special logic for 'γ' to cycle through four states
          minor_axis_arc=False
          current_index = button_states[particle_key]
          next_index = (current_index + 1) % len(self.g_states)
          button_states[particle_key] = next_index

          # Update the button description and color
          button.description = self.g_states[next_index]
          button.style.button_color = self.g_colors[next_index]

          # Update the plot based on the state
          if next_index == 0:  # γ
              ParticlePlotter.addParticleToPlot(Photon(), self.fig, minor_axis_arc=False)
          elif next_index == 1:  # γ̅
              ParticlePlotter.addParticleToPlot(AntiPhoton(), self.fig, minor_axis_arc=False)
          elif next_index == 2:  # G
              ParticlePlotter.addParticleToPlot(Graviton(), self.fig, minor_axis_arc=False)
          elif next_index == 3:  # G̅
              ParticlePlotter.addParticleToPlot(Graviton(), self.fig, minor_axis_arc=False)
      elif particle_key == "Z":
          minor_axis_arc=True
          if button_states[particle_key] > 0:
              button_states[particle_key] = -button_states[particle_key]
              wp, wm = StandardModelDemo.Z(particle=True)
              ParticlePlotter.addParticleToPlot(wp, self.fig, minor_axis_arc=minor_axis_arc)
              ParticlePlotter.addParticleToPlot(wm, self.fig, minor_axis_arc=minor_axis_arc)
              button.description = label
              button.style.button_color = color
          else:
              button_states[particle_key] = -button_states[particle_key]
              wm, wp = StandardModelDemo.Z(particle=False)
              ParticlePlotter.addParticleToPlot(wp, self.fig, minor_axis_arc=minor_axis_arc)
              ParticlePlotter.addParticleToPlot(wm, self.fig, minor_axis_arc=minor_axis_arc)
              button.description = anti_label
              button.style.button_color = anti_color

      else:
          # Default two-state toggle logic
          minor_axis_arc=False if particle_key in ("γ","g","G","ve","vmu","vtau",) else True
          if button_states[particle_key] > 0:
              button_states[particle_key] = -button_states[particle_key]
              ParticlePlotter.addParticleToPlot(particle_class(), self.fig, minor_axis_arc=minor_axis_arc)
              button.description = label
              button.style.button_color = color
          else:
              button_states[particle_key] = -button_states[particle_key]
              ParticlePlotter.addParticleToPlot(anti_particle_class(), self.fig, minor_axis_arc=minor_axis_arc)
              button.description = anti_label
              button.style.button_color = anti_color

      self.fig.show()  # Show the updated figure
    return
StandardModelDemo().display()


In [ ]:
from re import S
#@title BARYON STRINGS
from ipywidgets import Button,Dropdown, VBox, HBox, Layout, Output, Label
from IPython.display import display, HTML
from functools import partial
import plotly.graph_objects as go

class BaryonDemo(ParticleDemo):

  # Define the mapping of sorted combinations to knwon 1/2-spin baryon names
  baryon_map = {
      ("u", "u", "u") : "Δ⁺⁺",
      ("d", "d", "d") : "Δ⁻",
      ("d", "u", "u") : "p⁺",
      ("d", "d", "u") : "n",
      ("d", "s", "u") : "Λ⁰",
      ("c", "d", "u") : "Λc⁺",
      ("b", "d", "u") : "Λb⁰",
      ("s", "u", "u") : "Σ⁺",
      ("d", "s", "u") : "Σ⁰",
      ("d", "d", "s") : "Σ⁻",
      ("c", "u", "u") : "Σc⁺⁺",
      ("c", "d", "u") : "Σc⁺",
      ("c", "d", "d") : "Σc⁰",
      ("b", "u", "u") : "Σb⁺",
      ("b", "d", "u") : "Σb⁰",
      ("b", "d", "d") : "Σb⁻",
      ("s", "s", "u") : "Ξ⁰",
      ("d", "s", "s") : "Ξ⁻",
      ("c", "s", "u") : "Ξc⁺",
      ("c", "d", "s") : "Ξc⁰",
      ("c", "c", "u") : "Ξcc⁺⁺",
      ("c", "c", "d") : "Ξcc⁺",
      ("b", "s", "u") : "Ξb⁰",
      ("b", "d", "s") : "Ξb⁻",
      ("b", "b", "u") : "Ξbb⁰",
      ("b", "b", "d") : "Ξbb⁻",
      ("b", "c", "u") : "Ξcb⁺",
      ("b", "c", "d") : "Ξcb⁰",
      ("c", "s", "s") : "Ωc⁰",
      ("b", "s", "s") : "Ωb⁻",
      ("c", "c", "s") : "Ωcc⁺",
      ("b", "c", "s") : "Ωcb⁰",
      ("b", "b", "s") : "Ωbb⁻",
      ("b", "c", "c") : "Ωccb⁺",
      ("b", "b", "c") : "Ωcbb⁰",
  }

  # Define the mapping of sorted combinations to knwon 3/2-spin baryon names
  star_map = {
      ("u", "u", "u") : "Δ⁺⁺",
      ("d", "d", "d") : "Δ⁻",
      ("d", "u", "u") : "Δ⁺",
      ("d", "d", "u") : "Δ⁰",
      ("d", "s", "u") : "Λ*⁰",
      ("c", "d", "u") : "Λc*⁺",
      ("b", "d", "u") : "Λb*⁰",
      ("s", "u", "u") : "Σ*⁺",
      ("d", "s", "u") : "Σ*⁰",
      ("d", "d", "s") : "Σ*⁻",
      ("c", "u", "u") : "Σc*⁺⁺",
      ("c", "d", "u") : "Σc*⁺",
      ("c", "d", "d") : "Σc*⁰",
      ("b", "u", "u") : "Σb*⁺",
      ("b", "d", "u") : "Σb*⁰",
      ("b", "d", "d") : "Σb*-",
      ("s", "s", "u") : "Ξ*⁰",
      ("d", "s", "s") : "Ξ*⁻",
      ("c", "s", "u") : "Ξc*⁺",
      ("c", "d", "s") : "Ξc*⁰",
      ("c", "c", "u") : "Ξcc*⁺⁺",
      ("c", "c", "d") : "Ξcc*⁺",
      ("b", "s", "u") : "Ξb*⁰",
      ("b", "d", "s") : "Ξb*⁻",
      ("b", "b", "u") : "Ξbb*⁰",
      ("b", "b", "d") : "Ξbb*⁻",
      ("b", "c", "u") : "Ξcb*⁺",
      ("b", "c", "d") : "Ξcb*⁰",
      ("c", "s", "s") : "Ωc*⁰",
      ("b", "s", "s") : "Ωb*⁻",
      ("c", "c", "s") : "Ωcc*⁺",
      ("b", "c", "s") : "Ωcb*⁰",
      ("b", "b", "s") : "Ωbb*⁻",
      ("b", "c", "c") : "Ωccb*⁺",
      ("b", "b", "c") : "Ωcbb*⁰",
  }

  # Define the mapping of sorted combinations to knwon 1/2-spin and alternative 3/2-spin baryon names
  prime_map = {
      ("u", "u", "u") : "Δ⁺⁺",
      ("d", "d", "d") : "Δ⁻",
      ("d", "u", "u") : "Δ⁺",
      ("d", "d", "u") : "Δ⁰",
      ("d", "s", "u") : "Λ*⁰",
      ("c", "d", "u") : "Λc*⁺",
      ("b", "d", "u") : "Λb*⁰",
      ("s", "u", "u") : "Σ*⁺",
      ("d", "s", "u") : "Σ*⁰",
      ("d", "d", "s") : "Σ*⁻",
      ("c", "u", "u") : "Σc*⁺⁺",
      ("c", "d", "u") : "Σc*⁺",
      ("c", "d", "d") : "Σc*⁰",
      ("b", "u", "u") : "Σb*⁺",
      ("b", "d", "u") : "Σb*⁰",
      ("b", "d", "d") : "Σb*-",
      ("s", "s", "u") : "Ξ*⁰",
      ("d", "s", "s") : "Ξ*⁻",
      ("c", "s", "u") : "Ξc'⁺",
      ("c", "d", "s") : "Ξc'⁰",
      ("c", "c", "u") : "Ξcc*⁺⁺",
      ("c", "c", "d") : "Ξcc*⁺",
      ("b", "s", "u") : "Ξb'⁰",
      ("b", "d", "s") : "Ξb'⁻",
      ("b", "b", "u") : "Ξbb*⁰",
      ("b", "b", "d") : "Ξbb*⁻",
      ("b", "c", "u") : "Ξcb'⁺",
      ("b", "c", "d") : "Ξcb'⁰",
      ("c", "s", "s") : "Ωc*⁰",
      ("b", "s", "s") : "Ωb*⁻",
      ("c", "c", "s") : "Ωcc*⁺",
      ("b", "c", "s") : "Ωcb'⁰",
      ("b", "b", "s") : "Ωbb*⁻",
      ("b", "c", "c") : "Ωccb*⁺",
      ("b", "b", "c") : "Ωcbb*⁰",
  }

  def __init__(self):

    self.title = "Baryon strings"

    self.scene_camera = dict(eye=dict(x=0.5, y=0.3, z=0.5),center=dict(x=0,y=0,z=0.2))


    self.baryon_fig = go.Figure()
    self.prime_fig = go.Figure()
    self.star_fig = go.Figure()

    self.dropdowns = []
    self.selectedQuarks = ['u','u','d']

    for i in range(3):
        dd = Dropdown(options=[(f"{self.symbols[self.quarks[k]['color']]} {self.quarks[k]['label']}",k) for k in self.quarks.keys()], value=self.selectedQuarks[i], description=f'Quark {i+1}:')
        dd.observe(partial(self.on_quark_change,quark_index=i),names="value")
        self.dropdowns.append(dd)

    # Add labels for baryon names
    self.baryon_label = Label(value="Unknown", layout=Layout(width="100px"))
    self.prime_label = Label(value="Unknown", layout=Layout(width="100px"))
    self.star_label = Label(value="Unknown", layout=Layout(width="100px"))

    self.fig = BaryonDemo.dummy_fig()
    self.fig.show()  # Important for display
    self.refigure_layout()

    # Wrap the Plotly figures in Output widgets
    self.baryon_output = Output()
    self.prime_output = Output()
    self.star_output = Output()


    # Arrange the buttons in a row
    button_row = HBox(self.dropdowns, layout=Layout(align_items="center"))

    columns_row = [
        VBox([self.baryon_label, self.baryon_output],layout=self.columns_layout),
        VBox([self.prime_label, self.prime_output],layout=self.columns_layout),
        VBox([self.star_label, self.star_output],layout=self.columns_layout),
    ]

    # Combine the rows into a VBox
    self.ui = VBox([button_row,
        HBox(columns_row, layout=self.hbox_layout),
    ], layout=self.ui_layout)
    self.updateBaryons()


  def on_quark_change(self,change, quark_index):
    self.selectedQuarks[quark_index]=change.new
    self.updateBaryons()

  def refigure_layout(self):
      for figure in [self.fig, self.baryon_fig, self.prime_fig, self.star_fig]:
          self.apply_common_layout(figure)

  def getCurrentBaryon(self):
      """Create a baryon based on the current button states, display if valid."""

      # Get selected quarks and check validity

      quarks_combination = tuple(sorted(self.selectedQuarks))
      if quarks_combination in self.baryon_map:
          return Baryon(*[self.quarks[key]["quark"]() for key in quarks_combination])
      return None

  def getCurrentStar(self):
      """Create a baryon based on the current button states, display if valid."""

      # Get sorted combination of selected quarks
      quarks_combination = tuple(sorted(self.selectedQuarks))

      if quarks_combination in self.star_map:
          side_quarks = [self.quarks[key]["quark"]() for key in quarks_combination]

          star = Baryon(*side_quarks, mode=ClosedTetraParticle.mode_star)

          return star
      print("Unknown. Name to plot.")
      return None

  def getCurrentPrime(self):
      """Create a baryon based on the current button states, display if valid."""

      # Get sorted combination of selected quarks
      quarks_combination = tuple(sorted(self.selectedQuarks))

      if quarks_combination in self.prime_map:
          side_quarks = [self.quarks[key]["quark"]() for key in quarks_combination]

          prime = Baryon(*side_quarks, mode=ClosedTetraParticle.mode_prime)

          return prime
      print("Unknown. Name to plot.")
      return None

  def updateBaryons(self):
    current_baryon = self.getCurrentBaryon()
    current_prime = self.getCurrentPrime()
    current_star = self.getCurrentStar()

    quarks_combination = tuple(sorted(self.selectedQuarks))


    # Update the baryon labels
    if current_baryon:
        self.baryon_label.value = f"{self.baryon_map[quarks_combination]}"
    else:
        self.baryon_label.value = "Unknown"

    if current_prime:
        self.prime_label.value = f"{self.prime_map[quarks_combination]}"
    else:
        self.prime_label.value = "Unknown"

    if current_star:
        self.star_label.value = f"{self.star_map[quarks_combination]}"
    else:
        self.star_label.value = "Unknown"

    # Clear and update figures
    self.clear_and_update_figure(output=self.baryon_output,figure=self.baryon_fig,quark=current_baryon,add_quark_func=ParticlePlotter.addComplexParticleToPlot)
    self.clear_and_update_figure(output=self.prime_output,figure=self.prime_fig,quark=current_prime,add_quark_func=ParticlePlotter.addComplexParticleToPlot)
    self.clear_and_update_figure(output=self.star_output,figure=self.star_fig,quark=current_star,add_quark_func=ParticlePlotter.addComplexParticleToPlot)



BaryonDemo().display()

In [ ]:
#@title MESON STRINGS
from ipywidgets import Button,Dropdown, VBox, HBox, Layout, Output, Label
from IPython.display import display, HTML
from functools import partial
import plotly.graph_objects as go

class MesonDemo(ParticleDemo):

  # Define the mapping of sorted combinations to meson names
  pseudoscalar_map = {
      ("au", "d") : "π⁻",
      ("ad", "u") : "π⁺",
      ("ac", "c") : "ηc",
      ("ab", "b") : "ηb",
      ("as", "u") : "K⁺",
      ("au", "s") : "K⁻",
      ("as", "d") : "K⁰",
      ("ad", "s") : "K̅⁰",
      ("ad", "c") : "D⁺",
      ("ac", "d") : "D⁻",
      ("au", "c") : "D⁰",
      ("ac", "u") : "D̅⁰",
      ("as", "c") : "Dₛ⁺",
      ("ac", "s") : "Dₛ⁻",
      ("ab", "u") : "B⁺",
      ("au", "b") : "B⁻",
      ("ab", "d") : "B⁰",
      ("ad", "b") : "B̅⁰",
      ("ab", "s") : "Bₛ⁰",
      ("as", "b") : "B̅ₛ⁰",
      ("ab", "c") : "Bₛ⁺",
      ("ac", "b") : "Bₛ⁻",
  }

  pseudoscalar_super_map = {
      ("au", "d") : "π⁰",
      ("ad", "u") : "π⁰",
      ("ad", "s") : "K̅ₗ",
      ("as", "d") : "Kₗ",
  }

  scalar_map = {
      ("au", "d") : "σ",
      ("ad", "u") : "σ",
      ("ad", "s") : "K̅ₛ",
      ("as", "d") : "Kₛ",
  }

  vector_map = {
      ("au", "d") : "ρ⁻",
      ("ad", "u") : "ρ⁺",
      ("as", "s") : "ϕ",
      ("ac", "c") : "J/ψ",
      ("ab", "b") : "Υ",
      ("as", "u") : "K*⁺",
      ("au", "s") : "K*⁻",
      ("as", "d") : "K*⁰",
      ("ad", "s") : "K̅*⁰",
      ("ad", "c") : "D*⁺",
      ("ac", "d") : "D*⁻",
      ("au", "c") : "D*⁰",
      ("ac", "u") : "D̅*⁰",
      ("as", "c") : "Dₛ*⁺",
      ("ac", "s") : "Dₛ*⁻",
      ("ab", "u") : "B*⁺",
      ("au", "b") : "B*⁻",
      ("ab", "d") : "B*⁰",
      ("ad", "b") : "B̅*⁰",
      ("ab", "s") : "Bₛ*⁰",
      ("as", "b") : "B̅ₛ*⁰",
      ("ab", "c") : "Bₛ*⁺",
      ("ac", "b") : "Bₛ*⁻"
  }

  vector_super_map = {
      ("au", "d") : "ρ⁰",
      ("ad", "u") : "ρ⁰",
  }

  vector_sym_map = {
      ("au", "d") : "ω",
      ("ad", "u") : "ω",
  }



  # Define mappings between quarks and antiquarks
  quark_to_antiquark = {
      'u': 'au', 'd': 'ad', 'c': 'ac', 's': 'as', 't': 'at', 'b': 'ab'
  }
  antiquark_to_quark = {v: k for k, v in quark_to_antiquark.items()}

  def refigure_layout(self):
      # Apply common layout to all figures
      for figure in [self.fig, self.pseudoscalar_fig, self.pseudoscalar_super_fig, self.scalar_fig, self.vector_fig, self.vector_super_fig, self.vector_sym_fig]:
          self.apply_common_layout(figure)

  def __init__(self):
    self.scene_camera = dict(eye=dict(x=0.55, y=0.55, z=0.55),center=dict(x=0,y=0,z=0))
    self.title = "Meson strings"
    self.pseudoscalar_fig = go.Figure()
    self.pseudoscalar_super_fig = go.Figure()
    self.scalar_fig = go.Figure()

    self.vector_fig = go.Figure()
    self.vector_super_fig = go.Figure()
    self.vector_sym_fig = go.Figure()

    self.quark='d'
    self.antiquark='au'

    self.quark_dd = Dropdown(options=[(f"{MesonDemo.symbols[MesonDemo.quarks[k]['color']]} {MesonDemo.quarks[k]['label']}",k) for k in MesonDemo.quarks.keys()], value=self.quark, description='Quark:')
    self.antiquark_dd = Dropdown(options=[(f"{MesonDemo.symbols[MesonDemo.antiquarks[k]['color']]} {MesonDemo.antiquarks[k]['label']}",k) for k in MesonDemo.antiquarks.keys()], value=self.antiquark, description='Antiquark:')
    self.quark_dd.observe(self.on_quark_change,names="value")
    self.antiquark_dd.observe(self.on_antiquark_change,names="value")


    # Add labels for meson names
    self.pseudoscalar_label = Label(value="Unknown", layout=Layout(width="100px"))
    self.pseudoscalar_super_label = Label(value="Unknown", layout=Layout(width="100px"))
    self.scalar_label = Label(value="Unknown", layout=Layout(width="100px"))

    self.vector_label = Label(value="Unknown", layout=Layout(width="100px"))
    self.vector_super_label = Label(value="Unknown", layout=Layout(width="100px"))
    self.vector_sym_label = Label(value="Unknown", layout=Layout(width="100px"))

    self.fig = MesonDemo.dummy_fig()
    self.fig.show()  # Important for display
    self.refigure_layout()

    # Populate the Output widgets with the initial figures

    self.pseudoscalar_super_output = Output()
    self.pseudoscalar_output = Output()
    self.scalar_output = Output()

    self.vector_super_output = Output()
    self.vector_output = Output()
    self.vector_sym_output = Output()


    # Define the rows with both horizontal and vertical arrows


    button_row = HBox([self.quark_dd,self.antiquark_dd], layout=Layout(align_items="center"))


    columns_row1l = [
        VBox([self.pseudoscalar_super_label],layout=self.columns_layout),
        VBox([self.pseudoscalar_label],layout=self.columns_layout),
        VBox([self.scalar_label],layout=self.columns_layout),
    ]

    columns_row1 = [
        VBox([self.pseudoscalar_super_output],layout=self.columns_layout),
        VBox([self.pseudoscalar_output],layout=self.columns_layout),
        VBox([self.scalar_output],layout=self.columns_layout),
    ]

    columns_row2l = [
        VBox([self.vector_super_label],layout=self.columns_layout),
        VBox([self.vector_label],layout=self.columns_layout),
        VBox([self.vector_sym_label],layout=self.columns_layout)
    ]

    columns_row2 = [

        VBox([self.vector_super_output],layout=self.columns_layout),
        VBox([self.vector_output],layout=self.columns_layout),
        VBox([self.vector_sym_output],layout=self.columns_layout)
    ]

    # Combine the rows into a VBox
    self.ui = VBox([button_row,
        HBox(columns_row1l, layout=self.lbox_layout),
        HBox(columns_row1, layout=self.hbox_layout),
        HBox(columns_row2l, layout=self.lbox_layout),
        HBox(columns_row2, layout=self.hbox_layout),
    ], layout=self.ui_layout)
    self.update_mesons()
    # Display the UI





  def getCurrentPseudoscalar(self):
      """Create a pseudoscalar meson based on the current button states, display if valid."""

      # Get current quark and antiquark based on button states

      pair = tuple(sorted((self.quark, self.antiquark)))
      # Check for valid pseudoscalar meson
      if pair in MesonDemo.pseudoscalar_map:
          meson = PseudoscalarMeson(*[
              MesonDemo.quarks[self.quark]["quark"](), MesonDemo.antiquarks[self.antiquark]["antiquark"]()
          ])
          return meson

      return None

  def getCurrentPseudoscalarSuper(self):
      """Create a pseudoscalar meson based on the current button states, display if valid."""

      # Get selected quark and antiquark
      pair = tuple(sorted((self.quark, self.antiquark)))

      # Check for valid pseudoscalar super meson
      if pair in MesonDemo.pseudoscalar_super_map:
          if self.quark in ('u', 'd') and self.antiquark in ('au', 'ad'):
              if self.quark == 'u':
                  pair = (MesonDemo.quarks[self.quark]['quark'](), MesonDemo.antiquarks[MesonDemo.quark_to_antiquark[self.quark]]['antiquark']())
              else:
                  pair = (MesonDemo.quarks[MesonDemo.antiquark_to_quark[self.antiquark]]['quark'](), MesonDemo.antiquarks[self.antiquark]['antiquark']())
              meson = PseudoscalarMeson(*pair)
          else:
              pair = [MesonDemo.quarks[self.quark]["quark"](), MesonDemo.antiquarks[self.antiquark]["antiquark"]()]
  # old            pair = [antiquarks[antiquark]["antiquark"](), quarks[quark]["quark"]()]
              meson = PseudoscalarMeson(*pair)
          return meson
      return None

  def getCurrentScalar(self):
      """Create a scalar meson based on the current button states, display if valid."""

      # Get selected quark and antiquark
      pair = tuple(sorted((self.quark, self.antiquark)))

      # Check for valid scalar meson
      if pair in MesonDemo.scalar_map:
          if self.quark in ('u', 'd') and self.antiquark in ('au', 'ad'):
              pair = (MesonDemo.quarks[self.quark]['quark'](), MesonDemo.antiquarks[MesonDemo.quark_to_antiquark[self.quark]]['antiquark']()) if self.quark == 'u' else \
                  (MesonDemo.quarks[MesonDemo.antiquark_to_quark[self.antiquark]]['quark'](), MesonDemo.antiquarks[self.antiquark]['antiquark']())
              meson = PseudoscalarMeson(*pair)
          else:
  # old            pair = [quarks[quark]["quark"](), antiquarks[antiquark]["antiquark"]()]
              pair = [MesonDemo.antiquarks[self.antiquark]["antiquark"](), MesonDemo.quarks[self.quark]["quark"]()]
              meson = PseudoscalarMeson(*pair)
          return meson
      return None

  def getCurrentVector(self):
      """Create a VectorMeson based on the current button states, display if valid."""

      # Get selected quark and antiquark
      pair = tuple(sorted((self.quark, self.antiquark)))

      # Check for valid vector meson
      if pair in MesonDemo.vector_map:
          meson = VectorMeson(*[MesonDemo.quarks[self.quark]["quark"](), MesonDemo.antiquarks[self.antiquark]["antiquark"]()])

          return meson
      return None

  def getCurrentVectorSuper(self):
      """Create a VectorMeson antisymmetric superposition, rho0, based on the current button states, display if valid."""

      # Get selected quark and antiquark
      pair = tuple(sorted((self.quark, self.antiquark)))

      # Check for valid vector super meson
      if pair in MesonDemo.vector_super_map:
          pair = (MesonDemo.quarks[MesonDemo.antiquark_to_quark[self.antiquark]]['quark'](), MesonDemo.antiquarks[self.antiquark]['antiquark']())
          meson = VectorMeson(*pair, sup=True)

          return meson
      return None

  def getCurrentVectorSym(self):
      """Create a VectorMeson symmetric superposition, omega, based on the current button states, display if valid."""

      pair = tuple(sorted((self.quark, self.antiquark)))

      # Check for valid vector symmetric meson
      if pair in MesonDemo.vector_sym_map:
          if self.quark == 'u':
              pair = (MesonDemo.quarks[self.quark]['quark'](), MesonDemo.antiquarks[MesonDemo.quark_to_antiquark[self.quark]]['antiquark']())
          else:
              pair = (MesonDemo.quarks[MesonDemo.antiquark_to_quark[self.antiquark]]['quark'](), MesonDemo.antiquarks[self.antiquark]['antiquark']())
          meson = VectorMeson(*pair)

          return meson
      return None




  def on_quark_change(self,change):
    self.quark=change.new
    self.update_mesons()

  def on_antiquark_change(self,change):
    self.antiquark=change.new
    self.update_mesons()


  def update_mesons(self):

      current_pseudoscalar = self.getCurrentPseudoscalar()
      current_pseudoscalar_super = self.getCurrentPseudoscalarSuper()
      current_scalar = self.getCurrentScalar()

      current_vector = self.getCurrentVector()
      current_vector_super = self.getCurrentVectorSuper()
      current_vector_sym = self.getCurrentVectorSym()


      quark_antiquark_pair = (self.quark, self.antiquark)

      # Sort the combination to match the dictionary key format
      sorted_combination = tuple(sorted(quark_antiquark_pair))

      # Update the meson labels
      if current_pseudoscalar:
          self.pseudoscalar_label.value = f"{MesonDemo.pseudoscalar_map[sorted_combination]}"
          # Clear and update the pseudoscalar meson figure
          self.clear_figure(output=self.pseudoscalar_output,figure=self.pseudoscalar_fig)
          self.update_figure(output=self.pseudoscalar_output,figure=self.pseudoscalar_fig,quark=current_pseudoscalar,add_quark_func=ParticlePlotter.addComplexParticleToPlot,show_fig=True)
      else:
          self.pseudoscalar_output.clear_output(wait=False)
          self.pseudoscalar_label.value = "Unknown"

      if current_pseudoscalar_super:
          self.pseudoscalar_super_label.value = f"{MesonDemo.pseudoscalar_super_map[sorted_combination]}"
          # Clear and update the pseudoscalar superposition of mesons figure
          self.clear_figure(output=self.pseudoscalar_super_output,figure=self.pseudoscalar_super_fig)
          self.update_figure(output=self.pseudoscalar_super_output,figure=self.pseudoscalar_super_fig,quark=current_pseudoscalar_super,add_quark_func=ParticlePlotter.addComplexParticleToPlot,show_fig=False)
          if self.quark in ('u','d') and self.antiquark in ('au','ad'):
              if self.quark == 'u':
                  second_pair = (MesonDemo.antiquarks[self.antiquark]['antiquark'](),MesonDemo.quarks[MesonDemo.antiquark_to_quark[self.antiquark]]['quark']())  # Define how to retrieve this pair
              else:
                  second_pair = (MesonDemo.antiquarks[MesonDemo.quark_to_antiquark[self.quark]]['antiquark'](),MesonDemo.quarks[self.quark]['quark']())  # Define how to retrieve this pair
              pseudoscalar_meson = PseudoscalarMeson(*second_pair,sup=True)
          else:
              quark_antiquark_pair = (MesonDemo.quarks[MesonDemo.antiquark_to_quark[self.antiquark]]['quark'](), MesonDemo.antiquarks[MesonDemo.quark_to_antiquark[self.quark]]['antiquark']())
              pseudoscalar_meson = PseudoscalarMeson(*quark_antiquark_pair,sup=True)  # Bypass the default __init__ metho
          self.update_figure(output=self.pseudoscalar_super_output,figure=self.pseudoscalar_super_fig,quark=pseudoscalar_meson,add_quark_func=ParticlePlotter.addComplexParticleToPlot,show_fig=True)
      else:
          self.pseudoscalar_super_output.clear_output(wait=False)
          self.pseudoscalar_super_label.value = "Unknown"

      if current_scalar:
          self.scalar_label.value = f"{MesonDemo.scalar_map[sorted_combination]}"
          # Clear and update the scalar superpostion of mesons figure
          self.clear_figure(output=self.scalar_output,figure=self.scalar_fig)
          self.update_figure(output=self.scalar_output,figure=self.scalar_fig,quark=current_scalar,add_quark_func=ParticlePlotter.addComplexParticleToPlot,show_fig=False)
          if self.quark in ('u','d') and self.antiquark in ('au','ad'):
              if self.quark == 'u':
                  second_pair = (MesonDemo.quarks[MesonDemo.antiquark_to_quark[self.antiquark]]['quark'](),MesonDemo.antiquarks[self.antiquark]['antiquark']())  # Define how to retrieve this pair
              else:
                  second_pair = (MesonDemo.quarks[self.quark]['quark'](),MesonDemo.antiquarks[MesonDemo.quark_to_antiquark[self.quark]]['antiquark']())  # Define how to retrieve this pair
              scalar_meson = PseudoscalarMeson(*second_pair)  # Bypass the default __init__ method
          else:
              quark_antiquark_pair = (MesonDemo.quarks[MesonDemo.antiquark_to_quark[self.antiquark]]['quark'](), MesonDemo.antiquarks[MesonDemo.quark_to_antiquark[self.quark]]['antiquark']())
              scalar_meson = PseudoscalarMeson(*quark_antiquark_pair,sup=False)  # The default __init__ method
          self.update_figure(output=self.scalar_output,figure=self.scalar_fig,quark=scalar_meson,add_quark_func=ParticlePlotter.addComplexParticleToPlot,show_fig=True)
      else:
          self.scalar_output.clear_output(wait=False)
          self.scalar_label.value = "Unknown"

      if current_vector:
          self.vector_label.value = f"{MesonDemo.vector_map[sorted_combination]}"
          # Clear and update the vector meson figure
          self.clear_figure(output=self.vector_output,figure=self.vector_fig)
          self.update_figure(output=self.vector_output,figure=self.vector_fig,quark=current_vector,add_quark_func=ParticlePlotter.addComplexParticleToPlot,show_fig=True)
      else:
          self.vector_output.clear_output(wait=False)
          self.vector_label.value = "Unknown"

      if current_vector_super:
          self.vector_super_label.value = f"{MesonDemo.vector_super_map[sorted_combination]}"
          # Clear and update the vector meson figure
          self.clear_figure(output=self.vector_super_output,figure=self.vector_super_fig)
          self.update_figure(output=self.vector_super_output,figure=self.vector_super_fig,quark=current_vector_super,add_quark_func=ParticlePlotter.addComplexParticleToPlot,show_fig=False)

          second_pair = (MesonDemo.quarks[self.quark]['quark'](),MesonDemo.antiquarks[MesonDemo.quark_to_antiquark[self.quark]]['antiquark']())  # Define how to retrieve this pair
          vector_super = VectorMeson(*second_pair)
          self.update_figure(output=self.vector_super_output,figure=self.vector_super_fig,quark=vector_super,add_quark_func=ParticlePlotter.addComplexParticleToPlot,show_fig=True)
      else:
          self.vector_super_output.clear_output(wait=False)
          self.vector_super_label.value = "Unknown"

      if current_vector_sym:
          self.vector_sym_label.value = f"{MesonDemo.vector_sym_map[sorted_combination]}"
          # Clear and update the vector meson figure
          self.clear_figure(output=self.vector_sym_output,figure=self.vector_sym_fig)
          self.update_figure(output=self.vector_sym_output,figure=self.vector_sym_fig,quark=current_vector_sym,add_quark_func=ParticlePlotter.addComplexParticleToPlot,show_fig=False)
          if self.quark == 'u':
              second_pair = (MesonDemo.quarks[MesonDemo.antiquark_to_quark[self.antiquark]]['quark'](),MesonDemo.antiquarks[self.antiquark]['antiquark']())  # Define how to retrieve this pair
          else:
              second_pair = (MesonDemo.quarks[self.quark]['quark'](),MesonDemo.antiquarks[MesonDemo.quark_to_antiquark[self.quark]]['antiquark']())  # Define how to retrieve this pair
          vector_sym = VectorMeson(*second_pair)
          self.update_figure(output=self.vector_sym_output,figure=self.vector_sym_fig,quark=vector_sym,add_quark_func=ParticlePlotter.addComplexParticleToPlot,show_fig=True)
      else:
          self.vector_sym_output.clear_output(wait=False)
          self.vector_sym_label.value = "Unknown"


MesonDemo().display()

In [ ]:
#@title EXOTIC STRINGS (TETRA)
from ipywidgets import Button, VBox, HBox, Layout, Output, Label
from IPython.display import display, HTML
from functools import partial
import plotly.graph_objects as go

class SingleDropDownDemo(ParticleDemo):
  """
  Plot tetraquarks, hexaquarks, and an octaquark (Higgs) from corresponding map entry.
  In tetrahedral topology, a pentaquark is not a single string. Instead, a combined baryon and vector meson counts five quarks.
  """
  def __init__(self,combinations_map,title,dd_description,particleClass):
    self.combinations_map = combinations_map
    self.title = title
    self.particleClass = particleClass
    self.dd_description=dd_description
    self.scene_camera = dict(eye=dict(x=0.5, y=0.5, z=0.5),center=dict(x=0,y=0,z=0.2))
    # Create buttons
    initial_value = tuple(self.combinations_map.keys())[0]

    dd = Dropdown(options=[(f"{self.combinations_map[k]}",k) for k in self.combinations_map.keys()], value=initial_value, description=self.dd_description)
    dd.observe(self.on_value_change,names="value")


    # Initialize plot
    self.fig = SingleDropDownDemo.dummy_fig()
    self.fig.show()

    self.output = Output()

    # Display UI
    self.ui = VBox([
        HBox([dd], layout=Layout(align_items="center")),
        self.output
    ], layout=Layout(align_items="center"))


    self.updateParticle(initial_value)


  def refigure_layout(self):
      self.apply_common_layout(self.fig)

  def on_value_change(self,change):
    self.updateParticle(change.new)

  def updateParticle(self,combination):

    self.clear_and_update_figure(self.output, self.fig, self.getCurrentParticle(combination), ParticlePlotter.addComplexParticleToPlot)

  def getCurrentParticle(self,combination):
    quark_list = [(self.quarks[q]["quark"]() if q in self.quarks else self.antiquarks[q]["antiquark"]()) for q in combination]

    return self.particleClass(*quark_list)


SingleDropDownDemo({
      ("u", "au", "u", "au"): "X(uauuau)",
      ("d", "ad", "d", "ad"): "X(daddad)",
      ("u", "au", "c", "ac"): "X(uaucac)",
      ("d", "ad", "s", "as"): "X(dadsas)",
      ("ad", "d", "as", "s"): "X(addass)",
      ("s", "as", "u", "au"): "f0(980)",
      ("s", "as", "d", "au"): "a0(980)",
      ("c", "ac", "u", "au"): "X(3872)",
      ("c", "ac", "d", "ad"): "X(3872)",
      ("c", "ac", "s", "as"): "Y(4140)",
      ("c", "ac", "u", "ad"): "Zc(4430)",
      ("c", "ac", "d", "au"): "Zc(4430)",
      ("c", "ad", "c", "au"): "Tcc+",
      ("b", "ad", "b", "au"): "Tbb+",
      ("c", "as", "d", "au"): "?",
      ("c", "as", "u", "ad"): "?",
      ("b", "ab", "u", "ad"): "Zb(10610)",
      ("b", "ab", "d", "au"): "Zb(10610)",
  }, "Tetraquarks", "Tetraquark:",TetraQuark).display()

In [ ]:
#@title EXOTIC STRINGS (HEXA)

SingleDropDownDemo({
      ("u", "u", "u", "d", "d", "d") : "pn",

  }, "Hexaquarks", "Hexaquark:",HexaQuark).display()

In [ ]:
#@title EXOTIC STRINGS (OCTA)

SingleDropDownDemo({
      ("u", "au", "u", "au", "d", "ad", "d", "ad"):  "H(uu̅uu̅dd̅dd̅)",
      ("au", "u", "au", "u", "ad", "d", "ad", "d"): "(u̅uu̅ud̅dd̅d)"
  }, "Octaquarks", "Octaquark:",OctaQuark).display()

In [ ]:
#@title NUCLEI
""" Exemplifies some nuclei. Revise to meet your interest. """

import numpy as np
import plotly.graph_objects as go
from scipy.spatial.transform import Rotation as R
from ipywidgets import Button, Layout, HBox, VBox, Output, Label
from IPython.display import display, HTML

# Truncated tetrahedron
hexagon_side = np.sqrt(3)
tetrahedron_height = 2*np.sqrt(2)
scale_factor = hexagon_side/tetrahedron_height

# Basis vectors for the honeycomb lattice
v0 = np.array([0, 0, 0])
v1 = np.array([2, 0, 0])
v2 = np.array([-1, hexagon_side, 0])
v3 = np.array([-1, -hexagon_side, 0])
v4 = np.array([0, 0, tetrahedron_height])

# Dictionary of nucleon layers
l = {i: [i * v4] if i < 1 else [(i - 1) * v4] for i in range(-7, 8) if i != 0}

# Dictionary of neighboring nucleons in a layer with increasing distance from z-axis
d = {
    0: [v0],
    1: [v1, v2, v3],
    2: [v1 - v3, v2 - v3, v2 - v1, v3 - v1, v3 - v2, v1 - v2],
    3: [v1 + v2 - v3, -v1 + v2 + v3, v1 - v2 + v3],
    #4: [v1 + v2, v2 + v3, v3 + v1],
    4: [3 * v1, 3 * v2, 3 * v3],
    5: [2 * v1 - v3, 2 * v2 - v3, 2 * v2 - v1, 2 * v3 - v1, 2 * v3 - v2, 2 * v1 - v2],
    6: [v1 - v3 + v2 - v3, v2 - v1 + v3 - v1, v1 - v2 + v3 - v2],
    7: [v2 + 2 * (v1 - v3), v1 + 2 * (v2 - v3), v3 + 2 * (v2 - v1),
        v2 + 2 * (v3 - v1), v1 + 2 * (v3 - v2), v3 + 2 * (v1 - v2)],
    8: [2 * (v1 - v3), 2 * (v2 - v3), 2 * (v2 - v1), 2 * (v3 - v1), 2 * (v3 - v2), 2 * (v1 - v2)],
    9: [2*(v1 + v2 - v3), 2*(-v1 + v2 + v3), 2*(v1 - v2 + v3)],
    10: [2*(v1 - v3) + v2 - v3, 2*(v2 - v1) + v3 - v1, 2*(v3 - v2) + v1 - v2,
         v1 - v3 + 2*(v2 - v3), v2 - v1 + 2*(v3 - v1), v3 - v2 + 2*(v1 - v2)],
    11: [2*(v1 + v2 - v3) + v1 + v2, 2*(-v1 + v2 + v3) + v2 + v3, 2*(v1 - v2 + v3) + v3 + v1],
    12: [6 * v1, 6 * v2, 6 * v3],
}

def get_vertices():
    vertices = np.array([
            (3, 1, 1), (1, 3, 1), (1, 1, 3), (-3, -1, 1), (-1, -3, 1), (-1, -1, 3),
            (-3, 1, -1), (-1, 3, -1), (-1, 1, -3), (3, -1, -1), (1, -3, -1), (1, -1, -3)
        ]) * scale_factor
    return vertices

# Face definitions
hex_faces = [[1, 7, 8, 11, 9, 0], [6, 7, 1, 2, 5, 3], [5, 2, 0, 9, 10, 4], [3, 4, 10, 11, 8, 6]]
tri_faces = [[0, 1, 2], [3, 4, 5], [6, 7, 8], [9, 10, 11]]
tri_colors = ['lightgray', 'lightyellow', 'lightgray', 'lightgray'] # for building nuclei
hex_colors = ['white', 'lightcoral', 'plum', 'lightblue'] # for building nuclei

def getTetrahedron(flip, rot):
    vertices = get_vertices()

    # Tetrahedron dimensions
    tetrahedron_height = 2 * np.sqrt(2)
    tetrahedron_bottom = (3/4) * np.sqrt(2)
    even_offset = np.array([0, 0, tetrahedron_bottom])
    odd_offset = np.array([0, 0, tetrahedron_height - tetrahedron_bottom])

    # Define rotation matrices
    Axy = np.array([-1, 1, 0]) / np.sqrt(2)
    Rxy = R.from_rotvec((np.arccos(-1 / 3) / 2) * Axy).as_matrix()
    Rt = R.from_euler('z', np.pi / 12).as_matrix()
    Rz = R.from_euler('z', np.pi / 3).as_matrix()
    Rx = R.from_euler('x', np.pi).as_matrix()

    # Compute rotation matrices
    even_matrix = Rt @ Rxy
    even_alt_matrix = Rz @ even_matrix
    odd_alt_matrix = Rx @ even_matrix
    odd_matrix = Rz @ odd_alt_matrix
    odd_flip_matrix = Rx @ odd_matrix

    # Select the appropriate transformation to place a tetrahedron in a lattice point
    matrix = {
        (False, False): even_matrix,
        (False, True): even_alt_matrix,
        (True, False): odd_matrix,
        (True, True): odd_alt_matrix,
    }[(flip, rot)]

    # Apply transformation
    transformed_vertices =  vertices @ matrix.T

    # Apply offset
    offset = odd_offset if flip else even_offset

    return [transformed_vertices + offset]

def make_layer(tetrahedra, translation_vectors, layer, rot=False):
    translated_tetrahedra = []
    tri_angle = np.pi / 3
    Rz = R.from_euler('z', tri_angle).as_matrix()
    vectors=translation_vectors
    if rot:
       translation_vectors = [Rz @ v for v in vectors]
    for tetra in tetrahedra:
        for vector in translation_vectors:
            translated_tetrahedron = tetra + vector + layer  # Apply translation
            translated_tetrahedra.append(translated_tetrahedron)
    return [translated_tetrahedra]

def get_face_normal(face_vertices):
    """Computes a normal vector for a face using cross product of two edges."""
    v1 = face_vertices[1] - face_vertices[0]
    v2 = face_vertices[2] - face_vertices[0]
    normal = np.cross(v1, v2)
    return normal / np.linalg.norm(normal)  # Normalize

def get_orthonormal_basis(normal):
    """Finds two perpendicular vectors in the plane of the face."""
    arbitrary_vector = np.array([1, 0, 0]) if abs(normal[0]) < 0.95 else np.array([0, 1, 0])
    tangent1 = np.cross(normal, arbitrary_vector)
    tangent1 /= np.linalg.norm(tangent1)
    tangent2 = np.cross(normal, tangent1)
    return tangent1, tangent2

#Just append circle points into arc lists. plot everything together in the end.
def plot_circle_on_face(vertices, face, radius, color1, color2, scale_width, offset_angle, arcs_x=None, arcs_y=None, arcs_z=None,arc_colors=None):
    """Plots two circular arcs correctly aligned to a hexagonal face,
       with offset_angle dynamically adjusted relative to a reference vertex."""

    face_vertices = vertices[face]
    centroid = np.mean(face_vertices, axis=0)  # Compute centroid of hexagonal face

    normal = get_face_normal(face_vertices)
    tangent1, tangent2 = get_orthonormal_basis(normal)
    centroid = centroid - normal * 0.12

    ref_vertex = face_vertices[0]
    ref_vector = ref_vertex - centroid
    ref_vector /= np.linalg.norm(ref_vector)
    ref_angle = np.arctan2(np.dot(ref_vector, tangent2), np.dot(ref_vector, tangent1))

    offset = ref_angle + offset_angle

    # Define angles for two arcs of quarks
    angles1 = np.linspace(offset, offset + 2*np.pi/3, 30)  # 120-degree arc
    angles2 = np.linspace(offset + 2*np.pi/3, offset + 2*np.pi, 60)  # 240-degree arc

    # Compute first arc
    arc1_x = centroid[0] + radius * (np.cos(angles1) * tangent1[0] + np.sin(angles1) * tangent2[0])
    arc1_y = centroid[1] + radius * (np.cos(angles1) * tangent1[1] + np.sin(angles1) * tangent2[1])
    arc1_z = centroid[2] + radius * (np.cos(angles1) * tangent1[2] + np.sin(angles1) * tangent2[2])

    # Compute second arc
    arc2_x = centroid[0] + radius * (np.cos(angles2) * tangent1[0] + np.sin(angles2) * tangent2[0])
    arc2_y = centroid[1] + radius * (np.cos(angles2) * tangent1[1] + np.sin(angles2) * tangent2[1])
    arc2_z = centroid[2] + radius * (np.cos(angles2) * tangent1[2] + np.sin(angles2) * tangent2[2])

    if color1 is not None:
        width = 50 / scale_width**(1/4)
        #fig.add_trace(go.Scatter3d(x=arc1_x, y=arc1_y, z=arc1_z,mode='lines', line=dict(color=color1, width=width)))
        arcs_x.extend(arc1_x)
        arcs_y.extend(arc1_y)
        arcs_z.extend(arc1_z)

        arcs_x.append(np.nan)
        arcs_y.append(np.nan)
        arcs_z.append(np.nan)

        arc_colors.extend([color1]*(len(arc1_x)+1))
    if color2 is not None:
        width = 50 / scale_width**(1/4)
        #fig.add_trace(go.Scatter3d(x=arc2_x, y=arc2_y, z=arc2_z,mode='lines', line=dict(color=color2, width=width)))
        arcs_x.extend(arc2_x)
        arcs_y.extend(arc2_y)
        arcs_z.extend(arc2_z)

        arcs_x.append(np.nan)
        arcs_y.append(np.nan)
        arcs_z.append(np.nan)

        arc_colors.extend([color2]*(len(arc2_x)+1))

#Old version, keeping for backup for now
def plot_circle_on_face_OLD(vertices, face, radius, color1, color2, scale_width, offset_angle):
    """Plots two circular arcs correctly aligned to a hexagonal face,
       with offset_angle dynamically adjusted relative to a reference vertex."""

    face_vertices = vertices[face]
    centroid = np.mean(face_vertices, axis=0)  # Compute centroid of hexagonal face

    normal = get_face_normal(face_vertices)
    tangent1, tangent2 = get_orthonormal_basis(normal)
    centroid = centroid - normal * 0.12

    ref_vertex = face_vertices[0]
    ref_vector = ref_vertex - centroid
    ref_vector /= np.linalg.norm(ref_vector)
    ref_angle = np.arctan2(np.dot(ref_vector, tangent2), np.dot(ref_vector, tangent1))

    offset = ref_angle + offset_angle

    # Define angles for two arcs of quarks
    angles1 = np.linspace(offset, offset + 2*np.pi/3, 30)  # 120-degree arc
    angles2 = np.linspace(offset + 2*np.pi/3, offset + 2*np.pi, 60)  # 240-degree arc

    # Compute first arc
    arc1_x = centroid[0] + radius * (np.cos(angles1) * tangent1[0] + np.sin(angles1) * tangent2[0])
    arc1_y = centroid[1] + radius * (np.cos(angles1) * tangent1[1] + np.sin(angles1) * tangent2[1])
    arc1_z = centroid[2] + radius * (np.cos(angles1) * tangent1[2] + np.sin(angles1) * tangent2[2])

    # Compute second arc
    arc2_x = centroid[0] + radius * (np.cos(angles2) * tangent1[0] + np.sin(angles2) * tangent2[0])
    arc2_y = centroid[1] + radius * (np.cos(angles2) * tangent1[1] + np.sin(angles2) * tangent2[1])
    arc2_z = centroid[2] + radius * (np.cos(angles2) * tangent1[2] + np.sin(angles2) * tangent2[2])

    if color1 is not None:
        width = 50 / scale_width**(1/4)
        fig.add_trace(go.Scatter3d(x=arc1_x, y=arc1_y, z=arc1_z,
                                    mode='lines', line=dict(color=color1, width=width)))

    if color2 is not None:
        width = 50 / scale_width**(1/4)
        fig.add_trace(go.Scatter3d(x=arc2_x, y=arc2_y, z=arc2_z,
                                    mode='lines', line=dict(color=color2, width=width)))

#Plot tetra in single mesh and scatter plot instead of plotting every face and arc in separate plots. This should probably be further improved into plotting all tetras and arcs in single mesh3d and scatter3d
def plot_tetra(vertices, opacity=1.0, scale_width=20, nucleon='pn'):
    # Define color and offset angle mappings
    nucleon_mapping = {
        'pn': {
            'lightcoral':    ('blue', 'red', -5*np.pi/6),
            'lightblue':   ('blue', 'red', -np.pi/6),
            'plum': ('blue', 'red', -np.pi/2),
        },
        'nn': {
            'white':  (None, 'red', -5*np.pi/6 + np.pi/3),
            'lightcoral':    (None, 'blue', -5*np.pi/6 + 2*np.pi/3),
            'lightblue':   (None, 'red', -np.pi/6),
            'plum': (None, 'blue', -np.pi/2 - 2*np.pi/3),
        },
        'n': {
            'lightcoral':    ('blue', None, -5*np.pi/6),
            'lightblue':   ('blue', None, -np.pi/6),
            'plum': (None, 'red', -np.pi/2),
        },
        'p': {
            'lightcoral':    (None, 'red', -5*np.pi/6),
            'lightblue':   (None, 'red', -np.pi/6),
            'plum': ('blue', None, -np.pi/2),
        }
    }

    i = []
    j= []
    k = []
    face_colors = []
    arcs_x = []
    arcs_y = []
    arcs_z = []
    arc_colors = []

    for hi,hf in enumerate(hex_faces):
        i.append(hf[0])
        j.append(hf[1])
        k.append(hf[2])
        face_colors.append(hex_colors[hi])

        i.append(hf[0])
        j.append(hf[2])
        k.append(hf[5])
        face_colors.append(hex_colors[hi])

        i.append(hf[2])
        j.append(hf[3])
        k.append(hf[5])
        face_colors.append(hex_colors[hi])


        i.append(hf[3])
        j.append(hf[4])
        k.append(hf[5])
        face_colors.append(hex_colors[hi])


        # Plot circles on face if applicable
        if nucleon in nucleon_mapping and hex_colors[hi] in nucleon_mapping[nucleon]:
            color1, color2, offset_angle = nucleon_mapping[nucleon][hex_colors[hi]]
            plot_circle_on_face(vertices, hf, radius=1.3, color1=color1, color2=color2,
                                offset_angle=offset_angle, scale_width=scale_width, arcs_x=arcs_x, arcs_y=arcs_y, arcs_z=arcs_z,arc_colors=arc_colors)


    for ti,tf in enumerate(tri_faces):
        i.append(tf[0])
        j.append(tf[1])
        k.append(tf[2])

        face_colors.append(tri_colors[ti])
    tetra_plot = go.Mesh3d(
        x=vertices[:, 0], y=vertices[:, 1], z=vertices[:, 2],
        i=i,j=j,k=k,
        facecolor=face_colors,
        opacity=opacity,
        name =nucleon
    )
    fig.add_trace(tetra_plot)

    arc_plot = go.Scatter3d(
        x=arcs_x,
        y=arcs_y,
        z=arcs_z,
        mode='lines',
        line=dict(color=arc_colors, width = 50 / scale_width**(1/4)),
        name=nucleon)
    fig.add_trace(arc_plot)

    return



def plot_tetra_OLD(vertices, opacity=1.0, scale_width=20, nucleon='pn'):
    # Define color and offset angle mappings
    nucleon_mapping = {
        'pn': {
            'lightcoral':    ('blue', 'red', -5*np.pi/6),
            'lightblue':   ('blue', 'red', -np.pi/6),
            'plum': ('blue', 'red', -np.pi/2),
        },
        'nn': {
            'white':  (None, 'red', -5*np.pi/6 + np.pi/3),
            'lightcoral':    (None, 'blue', -5*np.pi/6 + 2*np.pi/3),
            'lightblue':   (None, 'red', -np.pi/6),
            'plum': (None, 'blue', -np.pi/2 - 2*np.pi/3),
        },
        'n': {
            'lightcoral':    ('blue', None, -5*np.pi/6),
            'lightblue':   ('blue', None, -np.pi/6),
            'plum': (None, 'red', -np.pi/2),
        },
        'p': {
            'lightcoral':    (None, 'red', -5*np.pi/6),
            'lightblue':   (None, 'red', -np.pi/6),
            'plum': ('blue', None, -np.pi/2),
        }
    }

    # Plot hexagonal faces
    for i, face in enumerate(hex_faces):
        face_vertices = vertices[face]
        fig.add_trace(go.Mesh3d(
            x=face_vertices[:, 0], y=face_vertices[:, 1], z=face_vertices[:, 2],
            color=hex_colors[i], opacity=opacity
        ))

        # Plot circles on face if applicable
        if nucleon in nucleon_mapping and hex_colors[i] in nucleon_mapping[nucleon]:
            color1, color2, offset_angle = nucleon_mapping[nucleon][hex_colors[i]]
            plot_circle_on_face(vertices, face, radius=1.3, color1=color1, color2=color2,
                                offset_angle=offset_angle, scale_width=scale_width)

    # Plot triangular faces
    for i, face in enumerate(tri_faces):
        face_vertices = vertices[face]
        fig.add_trace(go.Mesh3d(
            x=face_vertices[:, 0], y=face_vertices[:, 1], z=face_vertices[:, 2],
            color=tri_colors[i], opacity=opacity,
        ))

"""
def plot_nucleus(nucleus):
    num_tetrahedra=0
    fig.data = []
    for sublist in nucleus:
        for tetra in sublist:
            num_tetrahedra+=1
            plot_tetra(tetra, opacity=0.8)

    print("num_tetrahedra ",num_tetrahedra)
    fig.update_layout(scene=dict(aspectmode="data"))
    fig.show()
"""
TA = getTetrahedron(flip=False, rot=False)
TAR = getTetrahedron(flip=False, rot=True)
TB = getTetrahedron(flip=True, rot=False)
TBR = getTetrahedron(flip=True, rot=True)

# Define nuclear structure layer by layer l[] in range ...,-3,-2,-1,1,2,3,...
# In each layer list nucleons as d[:] in range 0,1,2,... with increasing distance from the symmetry z-axis.
# The order of l and n is important because tetrahedra are filled in the order pn, nn, n if n > p else pn, p.

N1p = [(TA, d[0], l[1], False)] # H-1
N1 = [(TA, d[0], l[1], False)] # H-2
N2 = [(TA, d[0], l[1], False), # He-4
      (TBR, d[0], l[-1], False)]
N8 = [(TB, d[0], l[1], False), # O-16
      (TA, d[1], l[1], True),
      (TAR, d[0], l[-1], False),
      (TBR, d[1], l[-1], True)]
N10 = N8 + [(TA, d[0], l[2], True), # Ne-20
            (TBR, d[0], l[-2], False)]
N12 = [(TA, d[1], l[1], False), # Mg-24
       (TB, d[1], l[1], True),
       (TAR, d[1], l[-1], True),
       (TBR, d[1], l[-1], False)]
N18 = N12 + [(TA, d[3], l[1], False), # Ar-36
             (TBR, d[3], l[-1], False)]
N16P = N12 + [(TA, d[1], l[2], True), # P-31
             (TB, d[0], l[2], False)]
N16 = N12 + [(TA, d[1], l[2], True), # S-32
             (TB, d[0], l[2], False)]
N20 = N12 + [(TA, d[1], l[2], True), # Ca-40
             (TB, d[0], l[2], False),
             (TBR, d[1], l[-2], True),
             (TAR, d[0], l[-2], False)]
N22 = N20 + [(TA, d[0], l[3], True), # Ca-42
             (TBR, d[0], l[-3], False)]
N26 = N18 + [(TB, d[0], l[2], False), # Cr-52
             (TA, d[1], l[2], True),
             (TAR, d[0], l[-2], False),
             (TBR, d[1], l[-2], True)]
N28 = N26 + [(TA, d[0], l[3], True), # Fe-56
             (TBR, d[0], l[-3], False)]
N24 = N18 + [(TB, d[3], l[1], True), # Ti-48
             (TAR, d[3], l[-1], True)]
N42 = N24 + [(TBR, d[1], l[2], False), # Sr-84
             (TAR, d[1], l[2], True),
             (TB, d[1], l[-2], True),
             (TA, d[1], l[-2], False),
             (TAR, d[3], l[2], True),
             (TB, d[3], l[-2], True)]
N36 = N24 + [(TA, d[5], l[1], False), # Ge-72
             (TBR, d[5], l[-1], False)]
N20Ar = [(TAR, d[0], l[1], False), # Ar-40
         (TB, d[0], l[-1], False),
         (TBR, d[1], l[1], True),
         (TA, d[1], l[-1], True),
         (TAR, d[2], l[1], False),
         (TB, d[2], l[-1], False)]
N20base = [(TB, d[0], l[1], False), # Ar-40
         (TAR, d[0], l[-1], False),
         (TA, d[1], l[1], True),
         (TBR, d[1], l[-1], True),
         (TB, d[2], l[1], False),
         (TAR, d[2], l[-1], False)]
N26alt = N20Ar + [(TAR, d[1], l[2], True),
                  (TB, d[1], l[-2], True)]
N26var = N20Ar + [(TBR, d[3], l[1], True), # Zn-64
                  (TA, d[3], l[-1], True)]
N32var = N26var + [(TAR, d[6], l[1], True), # Zn-64
                  (TB, d[6], l[-1], True)]
N50alt = N32var + [(TAR, d[1], l[2], True), # Sn-100
                  (TB, d[1], l[-2], True),
                  (TBR, d[1], l[2], False),
                  (TA, d[1], l[-2], False),
                  (TAR, d[3], l[2], True),
                  (TB, d[3], l[-2], True)]

N32 = N20base + [(TA, d[3], l[1], True), # Ni-64
             (TBR, d[3], l[-1], True)]
N38 = N32 + [(TB, d[6], l[1], True), # Ge-76
             (TAR, d[6], l[-1], True)]
N44 = N32 + [(TA, d[5], l[1], True), # Sr-88
             (TBR, d[5], l[-1], True)]
N50 = N44 + [(TB, d[6], l[1], True), # Sn-100
             (TAR, d[6], l[-1], True)]
N32alt = N20base + [(TBR, d[6], l[1], False), # To build on
             (TA, d[6], l[-1], False)]

N104alt=          [(TB, d[0], l[1], False),
               (TB, d[2], l[1], False),
               (TB, d[4], l[1], True),
               (TA, d[1], l[1], True),
               (TA, d[3], l[1], True),
               (TA, d[5], l[1], True),
               (TA, d[9], l[1], False),

               (TAR, d[0], l[-1], False),
               (TAR, d[2], l[-1], False),
               (TAR, d[4], l[-1], True),
               (TBR, d[1], l[-1], True),
               (TBR, d[3], l[-1], True),
               (TBR, d[5], l[-1], True),
               (TBR, d[9], l[-1], False),

               (TA, d[0], l[2], True),
               (TA, d[2], l[2], False),
               (TA, d[4], l[2], True),
               (TB, d[1], l[2], False),
               (TB, d[3], l[2], False),

               (TBR, d[0], l[-2], True),
               (TBR, d[2], l[-2], False),
               (TBR, d[4], l[-2], True),
               (TAR, d[1], l[-2], False),
               (TAR, d[3], l[-2], False),

               (TB, d[1], l[3], True),
               (TA, d[1], l[3], False),
               (TA, d[3], l[3], False),

               (TAR, d[1], l[-3], True),
               (TBR, d[1], l[-3], False),
               (TBR, d[3], l[-3], False),

               (TA, d[1], l[4], True),
               (TB, d[0], l[4], False),

               (TBR, d[1], l[-4], True),
               (TAR, d[0], l[-4], False),
               #(TA, d[0], l[7], False)
               ]

N104=          [(TB, d[0], l[1], False),
               (TB, d[2], l[1], False),
               (TB, d[4], l[1], True),
               (TA, d[1], l[1], True),
               (TA, d[3], l[1], True),
               (TA, d[5], l[1], True),
               #(TA, d[9], l[1], False),

               (TAR, d[0], l[-1], False),
               (TAR, d[2], l[-1], False),
               (TAR, d[4], l[-1], True),
               (TBR, d[1], l[-1], True),
               (TBR, d[3], l[-1], True),
               (TBR, d[5], l[-1], True),
               #(TBR, d[9], l[-1], False),

               (TA, d[0], l[2], True),
               (TA, d[2], l[2], False),
               (TA, d[4], l[2], True),
               (TB, d[1], l[2], False),
               (TB, d[3], l[2], False),

               (TBR, d[0], l[-2], True),
               (TBR, d[2], l[-2], False),
               (TBR, d[4], l[-2], True),
               (TAR, d[1], l[-2], False),
               (TAR, d[3], l[-2], False),

               (TB, d[1], l[3], True),
               (TA, d[1], l[3], False),
               (TA, d[3], l[3], False),

               (TAR, d[1], l[-3], True),
               (TBR, d[1], l[-3], False),
               (TBR, d[3], l[-3], False),

               (TA, d[1], l[4], True),
               (TB, d[0], l[4], False),

               (TBR, d[1], l[-4], True),
               (TAR, d[0], l[-4], False),

               (TA, d[0], l[5], False),

               (TBR, d[0], l[-5], False),
               ]
"""
nucleus_params = N24new
nucleus = sum([make_layer(T, V, H, rot) for T, V, H, rot in nucleus_params], [])
fig = go.Figure()
plot_nucleus(nucleus,N24new)
"""
# List of nuclei
nuclei_keys = ["N1p","N1","N2","N8","N10","N12","N16P","N16","N18","N20",
               "N22","N26","N26alt","N28","N24","N32","N36","N42","N44","N50alt","N50","N104"]  # Add more as needed
nuclei_map = {"N1p":N1p,"N1":N1,"N2":N2,"N8":N8,"N10":N10,"N12":N12,"N16P":N16P,"N16":N16,"N18":N18,"N20":N20,
              "N22":N22,"N26":N26,"N26alt":N26alt,"N28":N28,"N24":N24,"N32var":N32var,"N32":N32,
              "N36":N36,"N42":N42,"N44":N44,"N50alt":N50alt,"N50":N50,"N104":N104}
nuclei_names = {"N1p":"Hydrogen-1","N1":"Hydrogen-2","N2":"Helium-4","N8":"Oxygen-16","N10":"Neon-20","N12":"Magnesium-24",
    "N12g":"Oxygen-23","N16P":"Phosphorus-31","N16":"Sulfur-32","N18":"Argon-36","N20":"Calcium-40",
    "N22":"Calcium-44","N26":"Chromium-52","N26alt":"Chromium-52","N28":"Iron-56",
    "N24":"Calcium-42","N24":"Titanium-48","N32var":"Zinc-64","N32":"Nickel-64","N36":"Germanium-72","N38":"Germanium-76",
    "N42":"Strontium-84","N44":"Strontium-88","N50alt":"Tin-100","N50":"Tin-100","N104":"Lead-208",
    "N32var":"N38-76","N20base":"Argon-40","N20Ar":"Argon-40","N60alt":"New-80"}

def dummy_fig():
    return go.Figure().update_layout(
        width=50, height=50, xaxis_visible=False, yaxis_visible=False,
        scene=dict(xaxis=dict(visible=False), yaxis=dict(visible=False), zaxis=dict(visible=False)),
        margin=dict(l=0, r=0, t=0, b=0), paper_bgcolor='white', plot_bgcolor='white', showlegend=False)

# Initialize index and figure
current_index = 0
fig = go.Figure()
# Initialize plot
fig = dummy_fig()
fig.show()

output = Output()
num_tetrahedra_label = Label()
nucleus_name_label = Label()

def extract_Z_N(nucleus_name):
    elements = {
        "Neutron": 0,"Hydrogen": 1, "Helium": 2, "Lithium": 3, "Beryllium": 4, "Boron": 5, "Carbon": 6,
        "Nitrogen": 7, "Oxygen": 8, "Fluorine": 9, "Neon": 10, "Sodium": 11, "Magnesium": 12,
        "Aluminum": 13, "Silicon": 14, "Phosphorus": 15, "Sulfur": 16, "Chlorine": 17, "Argon": 18,
        "Potassium": 19, "Calcium": 20, "Scandium": 21, "Titanium": 22, "Vanadium": 23, "Chromium": 24,
        "Manganese": 25, "Iron": 26, "Cobalt": 27, "Nickel": 28, "Zinc": 30, "Germanium": 32,
        "Strontium": 38,"Tin": 50,"Mercury": 80, "Lead": 82
    }
    parts = nucleus_name.split("-")
    if len(parts) == 2:
        element, A = parts[0], int(parts[1])
        Z = elements.get(element, None)
        N = A - Z
        return Z, N
    return None, None

def plot_nucleus(nucleus, nucleus_key):
    nucleus_name = nuclei_names.get(nucleus_key, "Unknown")
    Z, N = extract_Z_N(nucleus_name) or (0, 100)
    # Ensure Z and N are not None
    if Z is None or N is None:
        Z, N = 0, 100

    A = Z + N
    neutron_excess = N - Z  # Neutron excess

    num_sublists = len(nucleus)  # Number of sublists in nucleus
    num_tetrahedra = sum(len(sublist) for sublist in nucleus)  # Total number of tetrahedra
    T = num_tetrahedra
    # Number of tetrahedra remaining after packing proton-neutron pairs
    remaining_tetrahedra = T - Z
    nn_tetrahedra = 0
    if neutron_excess > 0:
        n_tetrahedra = 2*remaining_tetrahedra % neutron_excess
        nn_tetrahedra = remaining_tetrahedra - n_tetrahedra
    fig.data = []  # Clear figure
    i = 0  # Counter for tetrahedra
    for sublist in nucleus:
        for tetra in sublist:
            if neutron_excess >= 0:
                if i < Z:
                    plot_tetra(tetra, opacity=0.5, scale_width=num_sublists, nucleon='pn')
                elif i < Z + nn_tetrahedra:
                    plot_tetra(tetra, opacity=0.5, scale_width=num_sublists, nucleon='nn')
                else:
                    plot_tetra(tetra, opacity=0.5, scale_width=num_sublists, nucleon='n')
            if neutron_excess < 0:
                if i < N:
                    plot_tetra(tetra, opacity=0.5, scale_width=len(nucleus),nucleon='pn')
                else:
                    plot_tetra(tetra, opacity=0.5, scale_width=len(nucleus),nucleon='p')
            i+=1

    fig.update_layout(title=f"{nucleus_key} - Number of tetrahedra: {num_tetrahedra}",
                      scene=dict(aspectmode="data"),
                      height=600, width=600,
                      showlegend=False)

    with output:
        output.clear_output(wait=True)
        fig.show()
    num_tetrahedra_label.value = f"Number of Tetrahedra: {num_tetrahedra}"
    nucleus_name_label.value = f"{nucleus_name} (Z={Z}, N={N})"

def navigate(direction):
    global current_index, label
    if direction == "next" and current_index < len(nuclei_keys) - 1:
        current_index += 1
    elif direction == "prev" and current_index > 0:
        current_index -= 1
    nucleus_params = nuclei_map[nuclei_keys[current_index]]
    nucleus = sum([make_layer(T, D, L, rot) for T, D, L, rot in nucleus_params], [])
    plot_nucleus(nucleus, nuclei_keys[current_index])
    label.value = nuclei_keys[current_index]

# Create buttons
prev_button = Button(description="←", layout=Layout(width="40px", height="40px"), style={"button_color": "lightgray"})
next_button = Button(description="→", layout=Layout(width="40px", height="40px"), style={"button_color": "lightgray"})

# Set button click events
prev_button.on_click(lambda _: navigate("prev"))
next_button.on_click(lambda _: navigate("next"))

# Initialize UI components
label = Label(value=nuclei_keys[current_index])
button_row = HBox([prev_button, next_button], layout=Layout(align_items="center"))
label_row = HBox([label], layout=Layout(align_items="center"))
nucleus_info_row = VBox([nucleus_name_label, num_tetrahedra_label], layout=Layout(align_items="center"))
ui = VBox([button_row, label_row, nucleus_info_row, output], layout=Layout(align_items="center", spacing="5px"))

# Initial plot
display(HTML('<span style="color: gray; font-size: 20px;">Nuclear Structure</span><br><br>'))
nucleus_params = nuclei_map[nuclei_keys[current_index]]
nucleus = sum([make_layer(T, D, L, rot) for T, D, L, rot in nucleus_params], [])
plot_nucleus(nucleus, nuclei_keys[current_index])
display(ui)


In [ ]:
#@title ISOTOPES
""" Shows some isotopes. """
# Zirconium-88 is radioactive nucleus with large neutron capture cross section
N48=          [(TA, d[0], l[1], True),
               (TA, d[2], l[1], False),
               (TB, d[1], l[1], False),

               (TBR, d[0], l[-1], True),
               (TBR, d[2], l[-1], False),
               (TAR, d[1], l[-1], False),

               (TB, d[1], l[2], True),
               (TA, d[1], l[2], False),

               (TAR, d[1], l[-2], True),
               (TBR, d[1], l[-2], False),

               (TA, d[1], l[3], True),
               (TB, d[0], l[3], False),

               (TBR, d[1], l[-3], True),
               (TAR, d[0], l[-3], False),

               (TA, d[0], l[4], False),

               (TBR, d[0], l[-4], False),
               (TB, d[3], l[1], False),
               (TAR, d[3], l[-1], False)
               ]
# Ytterbium-168-176 vary in shape as seen as shifts in mass and density in King plot
N88=          [(TB, d[0], l[1], False),
               (TB, d[2], l[1], False),
               (TB, d[4], l[1], True),
               (TA, d[1], l[1], True),
               (TA, d[3], l[1], True),
               (TA, d[5], l[1], True),

               (TAR, d[0], l[-1], False),
               (TAR, d[2], l[-1], False),
               (TAR, d[4], l[-1], True),
               (TBR, d[1], l[-1], True),
               (TBR, d[3], l[-1], True),
               (TBR, d[5], l[-1], True),

               (TA, d[0], l[2], True),
               (TA, d[2], l[2], False),
               #(TA, d[4], l[2], True),
               (TB, d[1], l[2], False),
               (TB, d[3], l[2], False),

               (TBR, d[0], l[-2], True),
               (TBR, d[2], l[-2], False),
               #(TBR, d[4], l[-2], True),
               (TAR, d[1], l[-2], False),
               (TAR, d[3], l[-2], False),

               (TB, d[1], l[3], True),
               (TA, d[1], l[3], False),
               (TA, d[3], l[3], False),

               (TAR, d[1], l[-3], True),
               (TBR, d[1], l[-3], False),
               (TBR, d[3], l[-3], False),
]
"""
               (TA, d[1], l[4], True),
               (TB, d[0], l[4], False),

               (TBR, d[1], l[-4], True),
               (TAR, d[0], l[-4], False),

               (TA, d[0], l[5], False),

               (TBR, d[0], l[-5], False),
"""
N104=          [(TB, d[0], l[1], False),
               (TB, d[2], l[1], False),
               (TB, d[4], l[1], True),
               (TA, d[1], l[1], True),
               (TA, d[3], l[1], True),
               (TA, d[5], l[1], True),

               (TAR, d[0], l[-1], False),
               (TAR, d[2], l[-1], False),
               (TAR, d[4], l[-1], True),
               (TBR, d[1], l[-1], True),
               (TBR, d[3], l[-1], True),
               (TBR, d[5], l[-1], True),

               (TA, d[0], l[2], True),
               (TA, d[2], l[2], False),
               #(TA, d[4], l[2], True),
               (TB, d[1], l[2], False),
               (TB, d[3], l[2], False),

               (TBR, d[0], l[-2], True),
               (TBR, d[2], l[-2], False),
               #(TBR, d[4], l[-2], True),
               (TAR, d[1], l[-2], False),
               (TAR, d[3], l[-2], False),

               (TB, d[1], l[3], True),
               (TA, d[1], l[3], False),
               (TA, d[3], l[3], False),

               (TAR, d[1], l[-3], True),
               (TBR, d[1], l[-3], False),
               (TBR, d[3], l[-3], False),

               (TA, d[1], l[4], True),
               (TB, d[0], l[4], False),

               (TBR, d[1], l[-4], True),
               (TAR, d[0], l[-4], False),

               (TA, d[0], l[5], False),

               (TBR, d[0], l[-5], False),
               (TA, d[4], l[2], True),
               (TBR, d[4], l[-2], True),
]
N102=          [(TB, d[0], l[1], False),
               (TB, d[2], l[1], False),
               (TB, d[4], l[1], True),
               (TA, d[1], l[1], True),
               (TA, d[3], l[1], True),
               (TA, d[5], l[1], True),

               (TAR, d[0], l[-1], False),
               (TAR, d[2], l[-1], False),
               (TAR, d[4], l[-1], True),
               (TBR, d[1], l[-1], True),
               (TBR, d[3], l[-1], True),
               (TBR, d[5], l[-1], True),

               (TA, d[0], l[2], True),
               (TA, d[2], l[2], False),
               #(TA, d[4], l[2], True),
               (TB, d[1], l[2], False),
               (TB, d[3], l[2], False),

               (TBR, d[0], l[-2], True),
               (TBR, d[2], l[-2], False),
               #(TBR, d[4], l[-2], True),
               (TAR, d[1], l[-2], False),
               (TAR, d[3], l[-2], False),

               (TB, d[1], l[3], True),
               (TA, d[1], l[3], False),
               (TA, d[3], l[3], False),

               (TAR, d[1], l[-3], True),
               (TBR, d[1], l[-3], False),
               (TBR, d[3], l[-3], False),

               (TA, d[1], l[4], True),
               (TB, d[0], l[4], False),

               (TBR, d[1], l[-4], True),
               (TAR, d[0], l[-4], False),

               #(TA, d[0], l[5], False),

               #(TBR, d[0], l[-5], False),
               (TA, d[4], l[2], True),
               (TBR, d[4], l[-2], True),
]
N100=          [(TB, d[0], l[1], False),
               (TB, d[2], l[1], False),
               (TB, d[4], l[1], True),
               (TA, d[1], l[1], True),
               (TA, d[3], l[1], True),
               (TA, d[5], l[1], True),

               (TAR, d[0], l[-1], False),
               (TAR, d[2], l[-1], False),
               (TAR, d[4], l[-1], True),
               (TBR, d[1], l[-1], True),
               (TBR, d[3], l[-1], True),
               (TBR, d[5], l[-1], True),

               (TA, d[0], l[2], True),
               (TA, d[2], l[2], False),
               #(TA, d[4], l[2], True),
               (TB, d[1], l[2], False),
               (TB, d[3], l[2], False),

               (TBR, d[0], l[-2], True),
               (TBR, d[2], l[-2], False),
               #(TBR, d[4], l[-2], True),
               (TAR, d[1], l[-2], False),
               (TAR, d[3], l[-2], False),

               (TB, d[1], l[3], True),
               (TA, d[1], l[3], False),
               (TA, d[3], l[3], False),

               (TAR, d[1], l[-3], True),
               (TBR, d[1], l[-3], False),
               (TBR, d[3], l[-3], False),

               #(TA, d[1], l[4], True),
               #(TB, d[0], l[4], False),

               #(TBR, d[1], l[-4], True),
               #(TAR, d[0], l[-4], False),

               #(TA, d[0], l[5], False),

               #(TBR, d[0], l[-5], False),
               (TA, d[4], l[2], True),
               (TBR, d[4], l[-2], True),

               (TBR, d[9], l[-1], False),
               (TA, d[9], l[1], False),
]
N98=          [(TB, d[0], l[1], False),
               (TB, d[2], l[1], False),
               (TB, d[4], l[1], True),
               (TA, d[1], l[1], True),
               (TA, d[3], l[1], True),
               (TA, d[5], l[1], True),

               (TAR, d[0], l[-1], False),
               (TAR, d[2], l[-1], False),
               (TAR, d[4], l[-1], True),
               (TBR, d[1], l[-1], True),
               (TBR, d[3], l[-1], True),
               (TBR, d[5], l[-1], True),

               (TA, d[0], l[2], True),
               (TA, d[2], l[2], False),
               #(TA, d[4], l[2], True),
               (TB, d[1], l[2], False),
               (TB, d[3], l[2], False),

               (TBR, d[0], l[-2], True),
               (TBR, d[2], l[-2], False),
               #(TBR, d[4], l[-2], True),
               (TAR, d[1], l[-2], False),
               (TAR, d[3], l[-2], False),

               (TB, d[1], l[3], True),
               (TA, d[1], l[3], False),
               (TA, d[3], l[3], False),

               (TAR, d[1], l[-3], True),
               (TBR, d[1], l[-3], False),
               (TBR, d[3], l[-3], False),

               (TA, d[1], l[4], True),
               (TB, d[0], l[4], False),

               (TBR, d[1], l[-4], True),
               (TAR, d[0], l[-4], False),

               (TA, d[0], l[5], False),

               (TBR, d[0], l[-5], False),
]
# List of nuclei
nuclei_keys = ["N98","N100","N102","N104","N88","N48"]  # Add more as needed
nuclei_map = {"N98":N98,"N100":N100,"N102":N102,"N104":N104,"N88":N88,"N48":N48}
nuclei_names = {"N98":"Ytterbium-168","N100":"Ytterbium-170","N102":"Ytterbium-172","N104":"Ytterbium-174","N88":"Ytterbium-176","N48":"Zirconium-88"}

current_index = 0
fig = go.Figure()
# Initialize plot
fig = dummy_fig()
fig.show()

output = Output()
num_tetrahedra_label = Label()
nucleus_name_label = Label()

def extract_Z_N(nucleus_name):
    elements = {
        "Zirconium": 40,"Ytterbium": 70
    }
    parts = nucleus_name.split("-")
    if len(parts) == 2:
        element, A = parts[0], int(parts[1])
        Z = elements.get(element, None)
        N = A - Z
        return Z, N
    return None, None

def plot_nucleus(nucleus, nucleus_key):
    nucleus_name = nuclei_names.get(nucleus_key, "Unknown")
    Z, N = extract_Z_N(nucleus_name) or (0, 100)
    # Ensure Z and N are not None
    if Z is None or N is None:
        Z, N = 0, 100

    A = Z + N
    neutron_excess = N - Z  # Neutron excess

    num_sublists = len(nucleus)  # Number of sublists in nucleus
    num_tetrahedra = sum(len(sublist) for sublist in nucleus)  # Total number of tetrahedra
    T = num_tetrahedra
    # Number of tetrahedra remaining after packing proton-neutron pairs
    remaining_tetrahedra = T - Z
    nn_tetrahedra = 0
    if neutron_excess > 0:
        n_tetrahedra = 2*remaining_tetrahedra % neutron_excess
        nn_tetrahedra = remaining_tetrahedra - n_tetrahedra
    fig.data = []  # Clear figure
    i = 0  # Counter for tetrahedra
    for sublist in nucleus:
        for tetra in sublist:
            if neutron_excess >= 0:
                if i < Z:
                    plot_tetra(tetra, opacity=0.5, scale_width=num_sublists, nucleon='pn')
                elif i < Z + nn_tetrahedra:
                    plot_tetra(tetra, opacity=0.5, scale_width=num_sublists, nucleon='nn')
                else:
                    plot_tetra(tetra, opacity=0.5, scale_width=num_sublists, nucleon='n')
            if neutron_excess < 0:
                if i < N:
                    plot_tetra(tetra, opacity=0.5, scale_width=len(nucleus),nucleon='pn')
                else:
                    plot_tetra(tetra, opacity=0.5, scale_width=len(nucleus),nucleon='p')
            i+=1

    fig.update_layout(title=f"{nucleus_key} - Number of tetrahedra: {num_tetrahedra}",
                      scene=dict(aspectmode="data"),
                      height=600, width=600,
                      showlegend=False)

    with output:
        output.clear_output(wait=True)
        fig.show()
    num_tetrahedra_label.value = f"Number of Tetrahedra: {num_tetrahedra}"
    nucleus_name_label.value = f"{nucleus_name} (Z={Z}, N={N})"

def navigate(direction):
    global current_index, label
    if direction == "next" and current_index < len(nuclei_keys) - 1:
        current_index += 1
    elif direction == "prev" and current_index > 0:
        current_index -= 1
    nucleus_params = nuclei_map[nuclei_keys[current_index]]
    nucleus = sum([make_layer(T, D, L, rot) for T, D, L, rot in nucleus_params], [])
    plot_nucleus(nucleus, nuclei_keys[current_index])
    label.value = nuclei_keys[current_index]

# Create buttons
prev_button = Button(description="←", layout=Layout(width="40px", height="40px"), style={"button_color": "lightgray"})
next_button = Button(description="→", layout=Layout(width="40px", height="40px"), style={"button_color": "lightgray"})

# Set button click events
prev_button.on_click(lambda _: navigate("prev"))
next_button.on_click(lambda _: navigate("next"))

# Initialize UI components
label = Label(value=nuclei_keys[current_index])
button_row = HBox([prev_button, next_button], layout=Layout(align_items="center"))
label_row = HBox([label], layout=Layout(align_items="center"))
nucleus_info_row = VBox([nucleus_name_label, num_tetrahedra_label], layout=Layout(align_items="center"))
ui = VBox([button_row, label_row, nucleus_info_row, output], layout=Layout(align_items="center", spacing="5px"))

# Initial plot
display(HTML('<span style="color: gray; font-size: 20px;">Nuclear Structure</span><br><br>'))
nucleus_params = nuclei_map[nuclei_keys[current_index]]
nucleus = sum([make_layer(T, D, L, rot) for T, D, L, rot in nucleus_params], [])
plot_nucleus(nucleus, nuclei_keys[current_index])
display(ui)

In [ ]:
#@title NEUTRON STAR CORE
""" Shows neutron-di-neutron-tetraquark lattice using functions from nuclei. """

dineutronstar = [(TA, d[0], l[1], False),
               (TA, d[2], l[1], False),
               (TA, d[4], l[1], False),
               (TA, d[6], l[1], False),
               (TA, d[8], l[1], True),

               (TB, d[1], l[1], False),
               (TB, d[3], l[1], False),
               (TB, d[5], l[1], False),
               (TB, d[7], l[1], False),

               (TA, d[1], l[2], False),
               (TA, d[3], l[2], False),
               (TA, d[5], l[2], False),
               (TA, d[7], l[2], False),

               (TB, d[1], l[2], True),
               (TB, d[3], l[2], True),
               (TB, d[5], l[2], True),
               (TB, d[9], l[2], False),

               (TB, d[0], l[3], False),
               (TB, d[2], l[3], False),
               (TB, d[4], l[3], True),
               (TA, d[1], l[3], True),
               (TA, d[3], l[3], True),
               (TA, d[5], l[3], True),
               (TA, d[9], l[3], False),

               (TA, d[0], l[4], True),
               (TA, d[2], l[4], False),
               (TA, d[4], l[4], True),
               (TB, d[1], l[4], False),
               (TB, d[3], l[4], False),

               (TB, d[1], l[5], True),
               (TA, d[1], l[5], False),
               (TA, d[3], l[5], False)]
neutronstar = dineutronstar + [
               (TA, d[12], l[1], True),
               (TB, d[11], l[1], False),
               (TA, d[10], l[1], False),
               (TA, d[11], l[2], False),
               (TA, d[1], l[6], True),
               (TB, d[0], l[6], False),
               (TA, d[0], l[7], False)]

# List of nuclei
nuclei_keys = ["neutronstar","dineutronstar"]  # Add more as needed
nuclei_map = {"neutronstar":neutronstar,"dineutronstar":dineutronstar}
nuclei_names = {"neutronstar":"Neutron-240","dineutronstar":"Neutron-240"}

current_index = 0
fig = go.Figure()
# Initialize plot
fig = dummy_fig()
fig.show()

output = Output()
num_tetrahedra_label = Label()
nucleus_name_label = Label()


def extract_Z_N(nucleus_name):
    elements = {
        "Neutron": 0,"Hydrogen": 1, "Helium": 2, "Lithium": 3, "Beryllium": 4, "Boron": 5, "Carbon": 6,
        "Nitrogen": 7, "Oxygen": 8, "Fluorine": 9, "Neon": 10, "Sodium": 11, "Magnesium": 12,
        "Aluminum": 13, "Silicon": 14, "Phosphorus": 15, "Sulfur": 16, "Chlorine": 17, "Argon": 18,
        "Potassium": 19, "Calcium": 20, "Scandium": 21, "Titanium": 22, "Vanadium": 23, "Chromium": 24,
        "Manganese": 25, "Iron": 26, "Cobalt": 27, "Nickel": 28, "Zinc": 30, "Germanium": 32, "Strontium": 38,"Tin": 50,"Mercury": 80
    }
    parts = nucleus_name.split("-")
    if len(parts) == 2:
        element, A = parts[0], int(parts[1])
        Z = elements.get(element, None)
        N = A - Z
        return Z, N
    return None, None

def plot_nucleus(nucleus, nucleus_key):
    nucleus_name = nuclei_names.get(nucleus_key, "Unknown")
    Z, N = extract_Z_N(nucleus_name) or (0, 100)
    # Ensure Z and N are not None
    if Z is None or N is None:
        Z, N = 0, 100

    A = Z + N
    neutron_excess = N - Z  # Neutron excess

    num_sublists = len(nucleus)  # Number of sublists in nucleus
    num_tetrahedra = sum(len(sublist) for sublist in nucleus)  # Total number of tetrahedra
    T = num_tetrahedra
    # Number of tetrahedra remaining after packing proton-neutron pairs
    remaining_tetrahedra = T - Z
    nn_tetrahedra = 0
    if neutron_excess > 0:
        n_tetrahedra = 2*remaining_tetrahedra % neutron_excess
        nn_tetrahedra = remaining_tetrahedra - n_tetrahedra
    fig.data = []  # Clear figure
    i = 0  # Counter for tetrahedra
    for sublist in nucleus:
        for tetra in sublist:
            if neutron_excess >= 0:
                if i < Z:
                    plot_tetra(tetra, opacity=0.5, scale_width=num_sublists, nucleon='pn')
                elif i < Z + nn_tetrahedra:
                    plot_tetra(tetra, opacity=0.5, scale_width=num_sublists, nucleon='nn')
                else:
                    plot_tetra(tetra, opacity=0.5, scale_width=num_sublists, nucleon='n')
            if neutron_excess < 0:
                if i < N:
                    plot_tetra(tetra, opacity=0.5, scale_width=len(nucleus),nucleon='pn')
                else:
                    plot_tetra(tetra, opacity=0.5, scale_width=len(nucleus),nucleon='p')
            i+=1

    fig.update_layout(title=f"{nucleus_key} - Number of tetrahedra: {num_tetrahedra}",
                      scene=dict(aspectmode="data"),
                      height=600, width=600,
                      showlegend=False)

    with output:
        output.clear_output(wait=True)
        fig.show()
    num_tetrahedra_label.value = f"Number of Tetrahedra: {num_tetrahedra}"
    nucleus_name_label.value = f"{nucleus_name} (Z={Z}, N={N})"

def navigate(direction):
    global current_index, label
    if direction == "next" and current_index < len(nuclei_keys) - 1:
        current_index += 1
    elif direction == "prev" and current_index > 0:
        current_index -= 1
    nucleus_params = nuclei_map[nuclei_keys[current_index]]
    nucleus = sum([make_layer(T, D, L, rot) for T, D, L, rot in nucleus_params], [])
    plot_nucleus(nucleus, nuclei_keys[current_index])
    label.value = nuclei_keys[current_index]

# Create buttons
prev_button = Button(description="←", layout=Layout(width="40px", height="40px"), style={"button_color": "lightgray"})
next_button = Button(description="→", layout=Layout(width="40px", height="40px"), style={"button_color": "lightgray"})

# Set button click events
prev_button.on_click(lambda _: navigate("prev"))
next_button.on_click(lambda _: navigate("next"))

# Initialize UI components
label = Label(value=nuclei_keys[current_index])
button_row = HBox([prev_button, next_button], layout=Layout(align_items="center"))
label_row = HBox([label], layout=Layout(align_items="center"))
nucleus_info_row = VBox([nucleus_name_label, num_tetrahedra_label], layout=Layout(align_items="center"))
ui = VBox([button_row, label_row, nucleus_info_row, output], layout=Layout(align_items="center", spacing="5px"))

# Initial plot
display(HTML('<span style="color: gray; font-size: 20px;">Neutron Star Core</span><br><br>'))
nucleus_params = nuclei_map[nuclei_keys[current_index]]
nucleus = sum([make_layer(T, D, L, rot) for T, D, L, rot in nucleus_params], [])
plot_nucleus(nucleus, nuclei_keys[current_index])
display(ui)

#**Reactions**:

In [ ]:
#@title ANIMATION OF THE NEAR-ANTENNA VACUUM

r"""
  ==============================================================================
  Animation of the Paired-Photon Vacuum near an Antenna
  Ref: Annila, E., & Annila, A. (2026). *Particles and Vacuum as Strings from
  the Quantum of Action.* Zenodo. https://doi.org/10.5281/zenodo.18669551

  ----------------------------------------------------------------------------

  What the animation shows

  In the ground state, the vacuum comprises rays of photons paired with
  opposite phases. Torsion along the rays manifests as an electric field and
  their coherent phases as a magnetic field. Accordingly, an oscillating
  antenna current twists and untwists the paired rays and winds and unwinds
  their phases.

  In the antenna animation, a trace displays the net ray torsion (color-coded
  handedness), corresponding to the electric field $E_\theta$, breathing with
  the dipole amplitude $|E(r,t)|$.

  The azimuthal phase of traces vortexing around the antenna corresponds to
  the magnetic field $B_\phi$. Circulating around the wire, the phase totals
  multiples of $2\pi$, giving $B_\phi = \mu_0 I / 2\pi r$.

  The phase lag $\Delta\Phi(r)$ between $E$ and $B$ is coded in a concentric
  color gradient.

  ----------------------------------------------------------------------------

  Field equations

  The oscillating dipole $p(t)=p_0\sin\omega t$ gives rise to the scalar and
  vector potentials

  \phi = \frac{p_0\cos\theta\, \omega}{4\pi\varepsilon_0 c}
  \left(\frac{\cos\omega t_r}{kr^2} - \frac{\sin\omega t_r}{r} \right)
  \qquad\qquad A_z = -\frac{\mu_0 p_0\omega}{4\pi}\frac{\sin\omega t_r}{r},

  with retarded time $t_r = t - r/c$ and wavenumber $k=\omega/c$. In the broad
  side plane, $\theta=\pi/2$, the fields $\mathbf{E} = -\nabla\phi - \partial\
  mathbf{A}/\partial t$ and $\mathbf{B} = \nabla\times\mathbf{A}$ reduce to:

  E_\theta = \frac{p_0 k^2 }{4\pi\varepsilon_0}
  \left(\underbrace{\frac{\cos\omega t_r}{k^2r^3}}_{\text{electrostatic}}
  +\underbrace{\frac{\sin\omega t_r}{kr^2}}_{\text{inductive}}
  -\underbrace{\frac{\cos\omega t_r}{r}}_{\text{radiative}}\right)

  B_\varphi = \frac{p_0k^2}{4\pi\varepsilon_0 c}
  \left(\underbrace{\frac{\sin\omega t_r}{kr^2}}_{\text{inductive}}
  +\underbrace{\frac{\cos\omega t_r}{r}}_{\text{radiative}}\right).

  Near field $kr\ll1$, the leading electric term $\sin\omega t_r/r^3$ and
  magnetic term $\cos\omega t_r/r^2$ are in quadrature. Energy sloshes
  reactively between capacitive torsion and inductive phase coherence with
  no net outward flow.

  At $kr=1$, the electric static and radiative terms cancel, while the
  inductive term is in phase with the magnetic inductive term. The phase lag
  is $\Delta\Phi=\arctan(1/kr)=45°$, halfway between reactive and radiative.

  Far field $kr\gg1$, the leading electric and magnetic components $\sin\omega
   t_r/r$ are in phase. Energy radiates.
  ==============================================================================
"""

# ── CELL 1: Imports ──────────────────────────────────────────────────────────
import numpy as np
import plotly.graph_objects as go
from plotly.subplots import make_subplots
from IPython.display import display

# ── CELL 2: Parameters ───────────────────────────────────────────────────────

# ── Tunable parameters ───────────────────────────────────────────────────────
AMPLITUDE      = .4      # helix radius scale (visual amplitude of torsion)
N_RADIAL_RAYS  = 8      # number of azimuthal ray directions (1,2,4,8,16)
N_WIRE_SAMPLES = 1      # number of wire source points along z (1,3,5,9)

# ── Fixed physical parameters ────────────────────────────────────────────────
c       = 1.0           # speed of light (normalised)
f       = 1.0           # antenna frequency
omega   = 2*np.pi*f
k       = omega/c
lam_w   = 2*np.pi/k     # wavelength = 1 in these units

R_MAX   = 2.0*lam_w     # radial extent of visualisation
N_HELIX = 120           # points per helix segment along ray
N_FRAMES= 48            # animation frames (two periods)
HELIX_TURNS = 1         # helix turns per wavelength (visual)

print(f'λ = {lam_w:.3f}  k = {k:.3f}  near/far boundary kr=1 at r = {1/k:.3f} = {1/k/lam_w:.3f}λ')
print(f'N_RADIAL_RAYS={N_RADIAL_RAYS}  N_WIRE_SAMPLES={N_WIRE_SAMPLES}  AMPLITUDE={AMPLITUDE}')


# ── CELL 3: Field functions ──────────────────────────────────────────────────

def E_field(R, t):
    """
    Full Hertzian-dipole electric field (theta component).
    Includes 1/R, 1/R^2, and 1/R^3 terms with correct phases.
    """
    tr = t - R / c
    kR = k * R

    # Far field (1/R)
    far = - np.cos(omega * tr) / R

    # Induction field (1/R^2)
    near =  np.sin(omega * tr) / (k*R**2)

    # Quasi-static field (1/R^3)
    verynear = np.cos(omega * tr) / (k**2*R**3)

    return far + near + verynear

def B_field(R, t):
    """
    Full Hertzian-dipole magnetic field (phi component).
    Includes 1/R and 1/R^2 terms with correct phases.
    """
    tr = t - R / c

    # Far field (1/R)
    far = np.sin(omega * tr) / R

    # Induction field (1/R^2)
    near = np.cos(omega * tr) / (k*R**2)

    return far + near

def phase_lag_deg(R):
    """Phase lag Δφ = arctan(1/kR) using full distance R."""
    return np.degrees(np.arctan(1.0 / (k * R + 1e-12)))


# Global amplitude normalisation: normalise to far-field amplitude at r=lam_w
_r_norm = lam_w
_E_scale = abs(np.sin(omega*0)/_r_norm)   # far-field scale
if _E_scale < 1e-9: _E_scale = 1.0

# print('Field functions defined.')


# ── CELL 4: Traces ───────────────────────────────────────────────

def make_ray_helix(az_angle, wire_z, t,
                   r_min=0.05, r_max=R_MAX,
                   n_pts=N_HELIX, amplitude=AMPLITUDE):
    """
    Photon-ray helix from wire source point (0, 0, wire_z).

    Continuity at torsion nodes
    ---------------------------
    At a node E(r,t)=0 the helix radius passes through zero. Both the
    outgoing and incoming half-cycles meet at the ray axis at that point,
    so the curve is already geometrically continuous there — no break needed.

    The key is a signed helix radius:
        helix_r_signed = amplitude * scale * tanh(E_vals * r_min * k)
    Because tanh is an odd function, helix_r_signed passes through zero
    smoothly and flips sign (= handedness) continuously. The helix then
    coils one way, tapers to zero, uncoils, passes through the axis, and
    recoils with opposite handedness — one single unbroken curve.

    Sampling
    --------
    Arc-length uniform spacing: concentrates points where the helix is
    tightly wound (large radius, near-field) and spreads them where it is
    nearly straight (small radius, at nodes or far-field).
    """
    ray_x  = np.cos(az_angle)
    ray_y  = np.sin(az_angle)
    E_ref  = 1.0 / lam_w   # far-field amplitude scale; fixes tanh saturation
    r_vals = np.geomspace(r_min, r_max, n_pts)

    # ── Field values on resampled grid ───────────────────────────────────────
    # Charge distribution: opposite sign at top and bottom
    sin_theta = r_vals / np.sqrt(r_vals**2 + wire_z**2 + 1e-9)
    # t_wire = t - wire_z / (lam_w * f)   # = t - wire_z / c, since lam_w * f = c
    t_wire = t - np.abs(wire_z) / c
    E_vals = E_field(r_vals, t_wire) * sin_theta
    B_vals = B_field(r_vals, t_wire) * sin_theta

    # ── Helix geometry: tanh-compressed signed radius ────────────────────────
    ramp = r_vals / (r_vals + r_min)
    helix_r_signed = amplitude * np.tanh(.1 * E_vals / E_ref) * ramp

    # ── Colour: log-compressed signed E for vivid far-field colour ───────────
    E_norm = np.tanh(E_vals / E_ref)

    # ── Helix structural phase ────────────────────────────────────────────────

    # ── Phase-plane rotation from B ──────────────────────────────────────────
    B_scale   = 1.0 / r_min
    B_log     = np.sign(B_vals) * np.log1p(np.abs(B_vals) / B_scale) / np.log(2)
    phi_plane = (np.pi / 2) * np.clip(B_log, -1, 1)

    # ── Transverse frame: fixed, no B-field rotation ─────────────────────────
    e1 = np.array([0.0, 0.0, 1.0])
    e2 = np.array([-ray_y, ray_x, 0.0])

    #helix_phase = 2*np.pi * HELIX_TURNS * r_vals / lam_w # no offset needed
    helix_phase = 2*np.pi * HELIX_TURNS * (r_vals - r_min) / lam_w

    cos_h = np.cos(helix_phase)
    sin_h = np.sin(helix_phase)
    offsets = (helix_r_signed[:,None]*cos_h[:,None]*e1[None,:] +
               helix_r_signed[:,None]*sin_h[:,None]*e2[None,:])

    core_x = r_vals * ray_x
    core_y = r_vals * ray_y
    core_z = np.full_like(r_vals, wire_z)

    x = core_x + offsets[:,0]
    y = core_y + offsets[:,1]
    z = core_z + offsets[:,2]

    # No NaN breaks — the signed-radius tanh ensures geometric continuity
    return x, y, z, E_norm, r_vals

# print('Helix geometry defined.')


#@ ── CELL 5: Distance scale ────────────────────────────────────────

def coherence_ring(r, t, n_az=64):
    """
    At radius r, draw a ring colored by the local phase lag.
    Near-field (lag ~90°) → orange/red
    Far-field  (lag ~0°)  → cyan/blue
    Returns x,y,z of ring and scalar lag in degrees.
    """
    phi_arr = np.linspace(0, 2*np.pi, n_az)
    x = r * np.cos(phi_arr)
    y = r * np.sin(phi_arr)
    z = np.zeros_like(phi_arr)
    lag = phase_lag_deg(r)
    return x, y, z, lag

# print('Coherence rings defined.')


# ── CELL 6: Build animation ─────────────────────────────────────────────

# Wire source points along z, spanning ±λ
#wire_z_vals = np.linspace(-lam_w, lam_w, N_WIRE_SAMPLES)
wire_z_vals = np.linspace(-lam_w/2, lam_w/2, N_WIRE_SAMPLES) if N_WIRE_SAMPLES > 1 else np.array([0.0])
#wire_z_vals = np.linspace(-lam_w/2, lam_w/2, N_WIRE_SAMPLES)

# Base azimuthal angles for rays
az_base = np.linspace(0, 2*np.pi, N_RADIAL_RAYS, endpoint=False)

# Coherence ring radii
ring_radii = np.array([0.125, 0.25, 0.5, 1.0, 2.0]) * lam_w

# Time steps: two full periods
t_vals = np.linspace(0, 2.0/f, N_FRAMES, endpoint=False)

def lag_to_color(lag_deg):
    """90 deg lag -> orange;  0 deg lag -> cyan."""
    frac = lag_deg / 90.0
    r = int(255 - 55 * (1 - frac))    # 255 → 200
    g = int(110 + 90 * (1 - frac))    # 110 → 200
    b = int(200 * (1 - frac))         #   0 → 200
    return f'rgb({r},{g},{b})'

def build_traces(t):
    traces = []

    # 1. Wire — Mesh3d cylinder, scales correctly with zoom
    _n_cyl = 24
    _r_cyl = 0.04 * lam_w
    _phi_c = np.linspace(0, 2*np.pi, _n_cyl, endpoint=False)
    _cx    = _r_cyl * np.cos(_phi_c)
    _cy    = _r_cyl * np.sin(_phi_c)
    # bottom ring, top ring, bottom centre, top centre
    _vx = np.concatenate([_cx, _cx, [0.0, 0.0]])
    _vy = np.concatenate([_cy, _cy, [0.0, 0.0]])
    _vz = np.concatenate([np.full(_n_cyl, -lam_w*0.6),
                          np.full(_n_cyl,  lam_w*0.6),
                          [-lam_w*0.6, lam_w*0.6]])
    _ii, _jj, _kk = [], [], []
    for _a in range(_n_cyl):
        _b = (_a + 1) % _n_cyl
        _ii += [_a, _a + _n_cyl, 2*_n_cyl,   2*_n_cyl+1]
        _jj += [_b, _b + _n_cyl, _a,          _a+_n_cyl]
        _kk += [_a+_n_cyl, _b,   _b,          _b+_n_cyl]
    traces.append(go.Mesh3d(
        x=_vx, y=_vy, z=_vz,
        i=_ii, j=_jj, k=_kk,
        color='#e05a00',
        opacity=0.2,
        showscale=False,
        name='Wire',
        showlegend=True,
        hoverinfo='skip',
    ))

    # 2. Coherence rings (horizontal circles at z=0)
    for ri, r_ring in enumerate(ring_radii):
        phi_arr = np.linspace(0, 2*np.pi, 128)
        rx = r_ring * np.cos(phi_arr)
        ry = r_ring * np.sin(phi_arr)
        rz = np.zeros_like(phi_arr)
        lag = phase_lag_deg(r_ring)
        col = lag_to_color(lag)
        traces.append(go.Scatter3d(
            x=rx, y=ry, z=rz,
            mode='lines',
            line=dict(color=col, width=4),
            name=f'r={r_ring/lam_w:.1f}\u03bb  \u0394\u03c6={lag:.0f}\u00b0',
            showlegend=(ri == 0 or ri == len(ring_radii)-1),
            legendgroup='rings'
        ))
    # 2. Semitransparent gradient disk: orange (inner,90°) → cyan (outer,0°)
    # Built as a filled Mesh3d using a polar grid of triangles.
    # Each radial shell is coloured by its phase lag arctan(1/kr).
    n_r_disk   = 60    # radial resolution
    n_az_disk  = 72    # azimuthal resolution
    r_disk_min = 0.05 * lam_w
    r_disk_max = R_MAX
    r_d   = np.linspace(r_disk_min, r_disk_max, n_r_disk)
    phi_d = np.linspace(0, 2*np.pi, n_az_disk, endpoint=False)
    RR, PP = np.meshgrid(r_d, phi_d, indexing='ij')
    Xd = (RR * np.cos(PP)).ravel()
    Yd = (RR * np.sin(PP)).ravel()
    Zd = np.zeros_like(Xd)

    # Colour each vertex by its phase lag
    lag_vals = np.degrees(np.arctan(1.0 / (k * r_d + 1e-9)))  # (n_r,)
    lag_grid = np.tile(lag_vals[:, None], (1, n_az_disk))       # (n_r, n_az)
    lag_flat = lag_grid.ravel()

    # Build triangulation: each cell (i,j)→(i+1,j)→(i,j+1) etc.
    i_tri, j_tri, k_tri = [], [], []
    for ri in range(n_r_disk - 1):
        for ai in range(n_az_disk):
            ai1 = (ai + 1) % n_az_disk
            p00 = ri  * n_az_disk + ai
            p10 = (ri+1) * n_az_disk + ai
            p01 = ri  * n_az_disk + ai1
            p11 = (ri+1) * n_az_disk + ai1
            i_tri += [p00, p10]
            j_tri += [p10, p01]
            k_tri += [p01, p11]

    # Vertex colours: orange with alpha = phase_lag/90
    # so the center (lag≈90°) is fully orange and the
    # outer edge (lag≈0°) fades to fully transparent.
    alpha_vals = np.clip(lag_flat / 90.0, 0, 1) * 0.55
    vertex_colors = [
        f'rgba(255,110,0,{a:.3f})' for a in alpha_vals
    ]
    traces.append(go.Mesh3d(
        x=Xd, y=Yd, z=Zd,
        i=i_tri, j=j_tri, k=k_tri,
        vertexcolor=vertex_colors,
        opacity=1.0,
        showscale=False,
        name='Phase lag disk',
        showlegend=True,
        hoverinfo='skip',
    ))

    # 3. Ray helices — each wire-z slice gets a distinct azimuthal offset
    #    so N_WIRE_SAMPLES * N_RADIAL_RAYS rays fan out without braiding.
    #    Offset = half a ray-spacing stepped across slices.
    ray_spacing = 2*np.pi / N_RADIAL_RAYS
    for wi, wz in enumerate(wire_z_vals):
        az_angles = az_base
        for az in az_angles:
            x, y, z, e_norm, r_vals = make_ray_helix(az, wz, t)

            # Phase lag per point: 1 at r_min (90°, gray), 0 at r_max (0°, full colour)
            # lag = np.arctan(1.0 / (k * r_vals + 1e-9)) / (np.pi/2)  # 0..1
            lag = np.exp(-k * r_vals)   # 1 at r=0, falls to near 0 by r=lambda/2pi

            # Torsion colour components
            e_c   = np.clip(e_norm, -1, 1)
            r_col = np.clip( e_c, 0, 1)   # positive → red
            b_col = np.clip(-e_c, 0, 1)   # negative → blue

            # Blend: lag=1 (near, 90°) → dark gray, lag=0 (far, 0°) → full colour
            gray  = 0.0
            r_f   = r_col * (1 - lag)
            g_f   = np.zeros_like(lag)
            b_f   = b_col * (1 - lag)
            point_colors = [
                f'rgb({int(r_f[i]*255)},{int(g_f[i]*255)},{int(b_f[i]*255)})'
                for i in range(len(e_norm))
            ]
            traces.append(go.Scatter3d(
                x=x, y=y, z=z,
                mode='lines',
                line=dict(color=point_colors, width=8),
                opacity=0.80,
                name='', showlegend=False
            ))
    """
    for wi, wz in enumerate(wire_z_vals):
        az_angles = az_base   # no stagger: all segments share the same azimuths
        for az in az_angles:
            x, y, z, e_norm = make_ray_helix(az, wz, t)
            traces.append(go.Scatter3d(
                x=x, y=y, z=z,
                mode='lines',
                line=dict(
                    color=e_norm,
                    colorscale=[
                        [0.0, 'rgb(0,50,200)'],    # Deep, highly visible blue
                        [0.45, 'rgb(50,80,150)'],
                        [0.5, 'rgb(40,40,40)'],     # Sharp charcoal gray exactly at E=0
                        [0.55, 'rgb(180,50,50)'],
                        [1.0, 'rgb(200,0,0)']       # Deep, highly visible red
                    ],
                    #colorscale=[[0,'rgb(0,0,200)'],[0.5,'rgb(0,0,0)'],[1,'rgb(200,0,0)']],
                    showscale=False,
                    cmin=-1.5, cmax=1.5,
                    width=4,
                ),
                opacity=0.80,
                name='', showlegend=False
            ))
    """
    return traces

# ── Initial frame ─────────────────────────────────────────────────────────────
init_traces = build_traces(t_vals[0])
fig = go.Figure(data=init_traces)

# ── Animation frames ──────────────────────────────────────────────────────────
frames = []
n_traces_per_frame = len(init_traces)
for i, t in enumerate(t_vals):
    frames.append(go.Frame(
        data=build_traces(t),
        name=str(i),
        traces=list(range(n_traces_per_frame))
    ))
fig.frames = frames

print(f'Built {len(frames)} frames, {n_traces_per_frame} traces each.')


# ── CELL 7: Layout and display ───────────────────────────────────────────────

axis_range = [-R_MAX*1.1, R_MAX*1.1]
z_range    = [-lam_w*1.3, lam_w*1.3]

fig.update_layout(
    title=dict(
        text=(
            f'Antenna Ray Trains — Near-field crowding (orange rings, decoherent) '
            f'→ Far-field coherence (cyan rings, in-phase)<br>'
            f'<sup>Helix color: red=RH torsion (E>0), blue=LH torsion (E<0)  |  '
            f'Ring color: orange=90° lag (reactive), cyan=0° lag (radiating)</sup>'
        ),
        font=dict(color='#111111', size=13, family='monospace'),
        x=0.02
    ),
    paper_bgcolor='white',
    plot_bgcolor ='white',
    scene=dict(
        bgcolor='white',
        xaxis=dict(visible=False, range=axis_range,
                   showgrid=False, showbackground=False, zeroline=False),
        yaxis=dict(visible=False, range=axis_range,
                   showgrid=False, showbackground=False, zeroline=False),
        zaxis=dict(visible=False, range=z_range,
                   showgrid=False, showbackground=False, zeroline=False),
        #aspectmode='manual',
        aspectratio=dict(x=1, y=1, z=0.8),
        #scene_camera = dict(projection=dict(type='perspective'))

        camera=dict(
            eye=dict(x=1.6, y=1.2, z=0.7),
            up=dict(x=0, y=0, z=1)
        )
    ),
    legend=dict(
        font=dict(color='#333333', size=9, family='monospace'),
        bgcolor='rgba(245,245,245,0.9)',
        bordercolor='#aaaaaa',
        x=0.01, y=0.99
    ),
    showlegend=True,
    margin=dict(l=0, r=0, t=80, b=0),
    height=700,
    updatemenus=[
        dict(
            type='buttons',
            showactive=False,
            y=0.02, x=0.12,
            xanchor='right',
            buttons=[
                dict(
                    label='▶ Play',
                    method='animate',
                    args=[None, dict(
                        frame=dict(duration=80, redraw=True),
                        fromcurrent=False,
                        transition=dict(duration=0)
                    )]
                ),
                dict(
                    label='⏸ Pause',
                    method='animate',
                    args=[[None], dict(
                        frame=dict(duration=0, redraw=False),
                        mode='immediate',
                        transition=dict(duration=0)
                    )]
                )
            ]
        ),
        dict(
            type='buttons',
            showactive=False,
            y=0.6, x=0.12,
            xanchor='right',
            buttons=[
                dict(
                    label='🔭 Overview',
                    method='relayout',
                    args=[{'scene.camera': dict(
                        eye=dict(x=1.4, y=1.0, z=0.6),
                        up=dict(x=0, y=0, z=1)
                    )}]
                ),
                dict(
                    label='🔬 Wire zoom',
                    method='relayout',
                    args=[{'scene.camera': dict(
                        eye=dict(x=0.25, y=0.18, z=0.10),
                        up=dict(x=0, y=0, z=1)
                    )}]
                ),
                dict(
                    label='🌐 Side view',
                    method='relayout',
                    args=[{'scene.camera': dict(
                        eye=dict(x=0.0, y=1.0, z=0.0),
                        up=dict(x=0, y=0, z=1)
                    )}]
                ),
                dict(
                    label='🌐 Side view zoom',
                    method='relayout',
                    args=[{'scene.camera': dict(
                        eye=dict(x=0.0, y=0.5, z=0.0),
                        up=dict(x=0, y=0, z=1)
                    )}]
                ),
                dict(
                    label='⬆ Top view',
                    method='relayout',
                    args=[{'scene.camera': dict(
                        eye=dict(x=0.0, y=0.0, z=0.8),
                        up=dict(x=1, y=0, z=0)
                    )}]
                ),
                dict(
                    label='⬆ Bottom view',
                    method='relayout',
                    args=[{'scene.camera': dict(
                        eye=dict(x=0.0, y=0.0, z=-0.8),
                        up=dict(x=1, y=0, z=0)
                    )}]
                ),
                dict(
                    label='⬆ Top view zoom',
                    method='relayout',
                    args=[{'scene.camera': dict(
                        eye=dict(x=0.0, y=0.0, z=0.25),
                        up=dict(x=1, y=0, z=0)
                    )}]
                ),
                dict(
                    label='⬆ Bottom view zoom',
                    method='relayout',
                    args=[{'scene.camera': dict(
                        eye=dict(x=0.0, y=0.0, z=-0.25),
                        up=dict(x=1, y=0, z=0)
                    )}]
                ),
            ]
        ),
    ],
    sliders=[dict(
        active=0,
        currentvalue=dict(
            prefix='Frame: ',
            font=dict(color='#333333', size=10)
        ),
        pad=dict(b=10, t=50),
        len=0.88, x=0.1, y=0.02,
        steps=[
            dict(
                args=[[str(i)], dict(
                    frame=dict(duration=80, redraw=True),
                    mode='immediate'
                )],
                label=f't={t_vals[i]/t_vals[-1]*2:.2f}T',
                method='animate'
            ) for i in range(N_FRAMES)
        ]
    )]
)

# Loop workaround: Plotly's loop=True is ignored in Colab's renderer.
# Instead: render via to_html, inject a small JS observer that restarts
# the animation each time the slider reaches the last frame.
from IPython.display import HTML, display

fig_html = fig.to_html(full_html=False, include_plotlyjs='cdn')

# Extract the div id so the JS can target it
import re as _re
_div_id = _re.search(r'id="([^"]+)"', fig_html).group(1)

loop_js = f"""
<script>
(function() {{
  var MAX_WAIT = 15000;   // ms to wait for Plotly to initialise
  var POLL    = 200;
  var waited  = 0;
  var divId   = '{_div_id}';
  var paused  = false;

  function tryAttach() {{
    var el = document.getElementById(divId);
    if (!el || !el._fullLayout) {{
      waited += POLL;
      if (waited < MAX_WAIT) setTimeout(tryAttach, POLL);
      return;
    }}

    el.on('plotly_animatingframe', function(e) {{
      // e.name is the frame name (stringified index)
      if (parseInt(e.name) === el._fullLayout._currentFrame
          || e.name === '{N_FRAMES - 1}') {{
        Plotly.animate(divId, null, {{
          frame: {{duration: 80, redraw: true}},
          transition: {{duration: 0}},
          fromcurrent: false
        }});
      }}
    }});

    // Intercept the Pause button click by watching plotly_buttonclicked
    el.on('plotly_buttonclicked', function(d) {{
      if (d && d.button && d.button.label === '\u23f8 Pause') {{
        paused = true;
      }}
      if (d && d.button && d.button.label === '\u25b6 Play') {{
        paused = false;
      }}
    }});


    // also listen for animation end
    el.on('plotly_animated', function() {{
      if (!paused) {{
        Plotly.animate(divId, null, {{
          frame: {{duration: 80, redraw: true}},
          transition: {{duration: 0}},
          fromcurrent: false
        }});
      }}
    }});
  }}
  setTimeout(tryAttach, POLL);
}})();
</script>
"""

display(HTML(fig_html + loop_js))
print('Animation rendered — press ▶ Play to start (loops automatically).')


Output hidden; open in https://colab.research.google.com to view.

In [ ]:
#@title ANIMATION OF ANNIHILATION
#TEST TRAIN OF GRAVITONS

class GravitonLine(ElementaryParticle):
    coilHandedness = ElementaryParticle.left_handedness
    windings = 1
    totalWindings = 1
    quanta=23
    name = "Photon"
    color = "black"

    def getHelix(self):
        t = np.linspace(0, -self.quanta*np.pi, get_num_helix_points(self.quanta))
        line = np.stack([np.zeros_like(t), np.zeros_like(t),t], axis=1)

        if self.position:
            line = fit_curve_to_position(self.position, line)

        return line


class GravitonWave(ElementaryParticle):
    coilHandedness = ElementaryParticle.left_handedness
    windings = 1
    totalWindings = 1
    quanta=23
    name = "Photon"
    color = "black"

    def getHelix(self):

        r = ElementaryParticle.spinRadius
        t = np.linspace(0, -self.quanta*np.pi, get_num_helix_points(self.quanta))
        wave = np.stack([np.zeros_like(t), self.coilHandedness * r * np.sin(t),t], axis=1)

        if self.position:
            wave = fit_curve_to_position(self.position, wave)

        return wave

class GravitonTrain(ElementaryParticle):
    coilHandedness = ElementaryParticle.left_handedness
    windings = 1
    totalWindings = 1
    quanta=23
    name = "Photon"
    color = "black"

    def getHelix(self):
        """
        Photon isn't a helix...
        """
        r = ElementaryParticle.spinRadius
        t = np.linspace(0, -self.quanta*np.pi, get_num_helix_points(self.quanta))

        wave1 = np.stack([np.zeros_like(t), self.coilHandedness * r * np.sin(t),t], axis=1)
        wave2 = np.stack([self.coilHandedness * r * np.sin(t), np.zeros_like(t),t], axis=1)
        wave3 = np.stack([np.zeros_like(t), -self.coilHandedness * r * np.sin(t),t], axis=1)
        wave4 = np.stack([-self.coilHandedness * r * np.sin(t), np.zeros_like(t),t], axis=1)

        train = np.concatenate([wave1, wave2, wave3, wave4], axis=0)

        if self.position:
            train = fit_curve_to_position(self.position, train)

        return train


class AnnihilationAnimation():

    plot_points_per_frame = 3

    def open_torus_pitch(*particles, start_pitch=0, end_pitch=Neutrino.spinRadius):
        """
        Returns frames for addining annihilation pitch to a torus
        """
        def _open_torus_pitch(particle:HelixParticle):
          n=20
          rng = np.linspace(start_pitch, end_pitch, n)
          frames = [{'helix':None,'quanta_offset':0}for i in rng]
          for i,pitch in enumerate(rng):
            particle.annihilationPitch = pitch
            frames[i]['helix'] = particle.getHelix()
          return frames

        return {p: _open_torus_pitch(p) for p in particles}

    def unwind(*particles:list,num_quanta=0):
        """
        Unwinds a helix particle into chain of photons.
        Args:
        num_quanta: how many quanta should be unwound.

        Returns:
        A dict with particles as keys and their frame data as values. Frame data consists of helix shape and quanta_offset (int)
        Quanta_offset is used for communicating how much of the first quanta in photon chain is still coiled up in particle.

        """
        num_quanta=num_quanta or max([p.quanta for p in particles])
        def _unwind(particle:HelixParticle):
            helix=particle.getHelix()

            gt1=GravitonWave()
            gt2=GravitonWave()
            gt3=GravitonWave()
            gt4=GravitonWave()
            gt5=GravitonLine()


            o=helix[-1] #Photon chain origin
            v=o-particle.position.origin #vector from particle origin to coil end.

            #turn 90 degrees
            v=R.from_rotvec(-particle.position.normalVector*(np.pi/2)).apply(v)

            v/=np.linalg.norm(v)
            graviton_pos=ParticlePosition(origin=o,#used to offset photon chain position to center of coil.
                                        rotationVector=v,
                                        normalVector=-particle.position.normalVector #Direction where chain should continue
                                        )




            rng=range(0,get_num_helix_points(num_quanta or particle.quanta),AnnihilationAnimation.plot_points_per_frame) # Range for generating frames
            d= {
                particle:[{
                    "helix":helix[i:],
                    "quanta_offset":0
                    }for i in rng],
                }
            gt_rot = R.from_rotvec(graviton_pos.normalVector*(np.pi / 2))
            for gi,gt in enumerate([gt1,gt2,gt3,gt4,gt5]):
              gt.setParticlePosition(graviton_pos)

              #rotate 90degrees
              graviton_pos.rotationVector = gt_rot.apply(graviton_pos.rotationVector)


              gt_points = gt.getHelix()
              d[gt]= [{
                    "helix":gt_points[max(i-get_num_helix_points(particle.quanta),0):i],
                    "quanta_offset":plot_resolution-i%plot_resolution #Photon quanta_offset should be a whole quante minus what is left of last quanta from particle.
                    }for i in rng]
            return d
        return {k: v for particle in particles for k, v in _unwind(particle).items()}

    def get_annihilation_frames(e:HelixParticle, p:HelixParticle):
          """
          Position particles with coil ends meeting and then unwind them

          """


          #Set particles parallel to eachoter
          nv=np.array([0,0,1],dtype=float)
          nv/=np.linalg.norm(nv)

          ov=np.array([1,0,0],dtype=float)
          ov/=np.linalg.norm(ov)

          o=np.array([0,0,-ElementaryParticle.spinRadius*2])
          e.setParticlePosition(ParticlePosition(
              origin=o,
              rotationVector=ov,
              normalVector=nv,
              anchor=ParticlePosition.anchor_end))
          p.setParticlePosition(ParticlePosition(
              rotationVector=ov,
              normalVector=nv,
              anchor=ParticlePosition.anchor_end))

          open_torus_frames = AnnihilationAnimation.open_torus_pitch(e,p)

          #Move positron down as torus opens, to get ends aligned.
          position_range = np.linspace(0,-p.spinRadius*2,len(open_torus_frames[p]))
          for i,translation in enumerate(position_range):
            open_torus_frames[p][i]['helix']+=p.position.normalVector*translation
          p.position.origin=e.position.origin

          unwind_frames = AnnihilationAnimation.unwind(e,p,num_quanta=20)
          frames = {particle:open_torus_frames[particle]+ unwind_frames[particle] for particle in [e,p]}

          graviton_waves= [particle for particle in unwind_frames.keys() if (isinstance(particle,GravitonWave) or isinstance(particle,GravitonLine))]

          for gt in graviton_waves:
            #insert as many empty frames as there is frames for opening toruses.
            graviton_frames = unwind_frames[gt]
            graviton_frames = [{
              "helix":np.array([np.array([0,0,0]),np.array([0,0,0.00001])]),
              "quanta_offset":0
              }]*len(open_torus_frames[p])+graviton_frames
            frames[gt] = graviton_frames

          return frames

    def showAnimation():
      global plot_resolution
      prev_plot_res = plot_resolution
      plot_resolution = 10
      particles = [Wminus(),Wplus()]

      #Fig has to be initialized with right types of data:
      # 1, main coil, 4 graviton waves and 1 graviton middle part

      fig = go.Figure(
          data=[go.Scatter3d(),go.Cone()]*len(particles)*4
      )

      #Add reaction frames to fig
      ParticlePlotter.animateParticleReaction(*particles,reaction_function=AnnihilationAnimation.get_annihilation_frames,fig=fig)

      plot_range = [-50, 50]
      slider_steps=70

      fig.update_layout(
          title="Test animations",
          showlegend=False,
          scene_camera=dict(eye=dict(x=-0.1, y=0.03, z=0.1),up=dict(x=-1,y=-1,z=0)),
          updatemenus=[
              {
                  "buttons": [
                      {
                          "args": [None, {'frame': {'duration': ParticlePlotter.frame_duration, 'redraw': True}, 'fromcurrent': True}],
                          "label": "Play",
                          "method": "animate",
                      },
                      {
                          "args": [[None], {'frame': {'duration': ParticlePlotter.frame_duration,}, 'mode': 'immediate'}],
                          "label": "Pause",
                          "method": "animate",
                      },

                  ],
                  "direction": "left",
                  "pad": {"r": 10, "t": 70},
                  "type": "buttons",
                  "x": 0.1,
                  "y": 0,
              }
          ],
          sliders = [{
              "pad": {"b": 10, "t": 60},
              "len": 0.9,
              "x": 0.1,
              "y": 0,

              "steps": [
                          {"args": [[f.name], {'frame': {'duration': ParticlePlotter.frame_duration, 'mode': 'immediate'}, 'mode': 'immediate'}],
                          "label": "Annihilate" if k==21 else ("Open torus pitch" if k==0 else str(k)),
                          "method": "animate",
                          } for k, f in [[i,fig.frames[i]] for i in np.linspace(0, len(fig.frames)-1, slider_steps, dtype=int)]
                      ]
          }],
          scene={
              "xaxis": {
                  "visible":False,
                  "title": "X Axis",
                  "range": plot_range,
                  "autorange":False
              },
              "yaxis": {
                  "visible":False,
                  "title": "Y Axis",
                  "range": plot_range,
                  "autorange":False
              },
              "zaxis": {
                  "visible":False,
                  "title": "Z Axis",
                  "range": plot_range,
                  "autorange":False
              }
          }
      )



      fig.layout.scene.aspectratio = {'x':1, 'y':1, 'z':1}
      plot_resolution = prev_plot_res
      fig.show()
AnnihilationAnimation.showAnimation()

Output hidden; open in https://colab.research.google.com to view.

In [ ]:
#@title ANNIHILATION
from ipywidgets import Button, VBox, HBox, Layout, Output, Label, HTML
from IPython.display import display
import plotly.graph_objects as go


class AnnihilationDemo(ParticleDemo):

  def getOriginBelow():
      return np.array([0,0,-ElementaryParticle.spinRadius*2])



  # Populate figures for electron-positron annihilation
  def populate_figures(self):

      outputs = []
      for i, (label, pair) in enumerate(zip(self.labels, self.particles)):
          output = Output()
          fig = go.Figure()
          for particle in pair:
              # Check if the particle is a train
              if isinstance(particle, GravitonTrain):
                  ParticlePlotter.addParticleToPlot(particle, fig, minor_axis_arc=False)
              elif isinstance(particle, ComplexParticle3):
                  ParticlePlotter.addComplexParticleToPlot(particle, fig, minor_axis_arc=True)
                  #commented out adding triangles. Triangles not shown anywhere else either (Baryons for example)
                  #ParticlePlotter.addTriangleStructureToPlot(particle.triangles,fig)
              else:
                  ParticlePlotter.addParticleToPlot(particle, fig, minor_axis_arc=True)
          self.apply_common_layout(fig)
          with output:
              display(fig)
          outputs.append(VBox([Label(value=label), output], layout=Layout(align_items="center")))

      return outputs

  # Create the UI
  def create_ui(self):
      columns = self.populate_figures()
      horizontal_arrow = HTML(value='<span style="font-size: 24px; color: gray;">&#x2192;</span>')
      column_layout = [columns[0], horizontal_arrow, columns[1], horizontal_arrow, columns[2]]
      self.ui = VBox([
          HBox(column_layout, layout=Layout(justify_content="center", gap="20px"))
      ], layout=Layout(align_items="center", spacing="5px"))


  def __init__(self):
    self.scene_camera=dict(eye=dict(x=.5, y=.5, z=1.0))

    fig = AnnihilationDemo.dummy_fig()
    fig.show()  # Important for display

    self.apply_common_layout(fig)

    self.create_ui()

class ElectronPositronAnnihilationDemo(AnnihilationDemo):
  def __init__(self):
    self.title="Electron-positron annihilation"
    self.labels = ["e⁺ + e⁻", "W⁺ + W⁻", "annihilating"]
    self.particles = [
          [ElectronPositronAnnihilationDemo.getElectron(), ElectronPositronAnnihilationDemo.getPositron()],
          [ElectronPositronAnnihilationDemo.getWminus(), ElectronPositronAnnihilationDemo.getWplus()],
          [ElectronPositronAnnihilationDemo.getAntiUp(), ElectronPositronAnnihilationDemo.getUp(), ElectronPositronAnnihilationDemo.getTrain()]
      ]

    super().__init__()

  def getTrainStart():
      return np.array([-HelixParticle.torusRadius,0,-ElementaryParticle.spinRadius*0])

  def getUpperPosition():
      return ParticlePosition(
          anchor=ParticlePosition.anchor_end,
          rotationVector=np.array([1,0,0]),
          normalVector=np.array([0,0,1]),
      )

  # Define particle creation functions
  def getElectron():
      e=Electron()
      pos = ElectronPositronAnnihilationDemo.getUpperPosition()
      pos.origin=AnnihilationDemo.getOriginBelow()
      e.setParticlePosition(pos)
      return e

  def getWminus():
      wm=Wminus()
      pos = ElectronPositronAnnihilationDemo.getUpperPosition()

      wm.setParticlePosition(pos)
      wm.annihilationPitch = wm.helixRadius
      return wm

  def getAntiUp():
      au=AntiUp()
      pos = ElectronPositronAnnihilationDemo.getUpperPosition()

      au.setParticlePosition(pos)
      au.annihilationPitch = au.helixRadius
      return au

  def getPositron():
      p=Positron()
      pos = ElectronPositronAnnihilationDemo.getUpperPosition()
      p.setParticlePosition(pos)
      return p

  def getWplus():
      wp=Wplus()
      pos = ElectronPositronAnnihilationDemo.getUpperPosition()
      wp.setParticlePosition(pos)
      wp.annihilationPitch = wp.helixRadius
      return wp

  def getUp():
      up=Up()
      pos = ElectronPositronAnnihilationDemo.getUpperPosition()
      up.setParticlePosition(pos)
      up.annihilationPitch = up.helixRadius
      return up


  def getTrain():
      offset = ParticlePosition(
          origin=np.array([-HelixParticle.torusRadius-ElementaryParticle.spinRadius, 0, 0]),
          normalVector=np.array([0,0,-1]))
      train=GravitonTrain()
      train.position=offset

      return train
ElectronPositronAnnihilationDemo().display()


HTML(value='<span style="color: gray; font-size: 20px;">Electron-positron annihilation</span><br><br>')

In [ ]:
#@title ELECTRON CAPTURE
from ipywidgets import Button, VBox, HBox, Layout, Output, Label, HTML
from IPython.display import display, HTML
from functools import partial
import plotly.graph_objects as go  # Assuming you're using Plotly
from ipywidgets import HTML

"""
Plot steps of electron capture.
"""

class ProtonCut(OpenTetraParticle,ComplexParticle3):
    def __init__(self):
        ad=AntiDown()
        up=Up()
        down=Down()
        sequence=[0,2,1]

        super().__init__([ad, up, down],sequence,mode=TetraParticle.mode_normal)

        prot = Proton()
        mo=prot.sides[0].position.minorOrientation

        a,b,c,d=self.points
        ac,bc,cc,dc=self.centers
        offset_ac=np.array([0,0,0*0.667*ElementaryParticle.spinRadius])
        ad.setParticlePosition(ParticlePosition(

# OFFSET DUE TO ANNIHILATION
            origin=ac-offset_ac,
            rotationVector=np.array(ac-c),
#            rotationVector=np.array(ac-b),
            normalVector=np.array(d-ac),
            anchor=ParticlePosition.anchor_opening,
            minorOrientation=-mo
        ))
        ad.annihilationPitch=0
        up.setParticlePosition(ParticlePosition(
            origin=bc,
            rotationVector=np.array(a-bc),
            normalVector=np.array(c-bc),
            anchor=ParticlePosition.anchor_opening,
            minorOrientation=-mo
        ))
        down.setParticlePosition(ParticlePosition(
            origin=cc,
            rotationVector=np.array(cc-a),
            normalVector=np.array(b-cc),
            anchor=ParticlePosition.anchor_opening,
            minorOrientation=mo
        ))

        self.reverse=True
        self.gluons=[Gluon(particleA=ad,particleB=down),Gluon(particleA=down,particleB=up)]

class ElectronCaptureDemo(AnnihilationDemo):

  # Particle setup
  def getProton(): return Baryon(Up(), Down(), Up())
  def getNeutron(): return Baryon(Down(), Down(), Up() )

  def getBasePosition(base_quark):
      #Get direction of bottom quark end. Should add transformations between different anchor positions to ParticlePosition
      rv = base_quark.position.origin-base_quark.getMinorAxisArc()[-1]

      #Set wminus position so that end of it's coil is aligned towards bottom quark end
      return ParticlePosition(
          origin=AnnihilationDemo.getOriginBelow(),
          anchor=ParticlePosition.anchor_end,
          rotationVector=rv,
          normalVector=np.array([0,0,1]),
      )
  def getWminus():
      wm = Wminus()
      base_quark=ElectronCaptureDemo.getProton().sides[0]
      wm.setParticlePosition(ElectronCaptureDemo.getBasePosition(base_quark))

      return wm

  def getAntiUp():
      au = AntiUp()
      base_quark=ElectronCaptureDemo.getProtonCut().sides[0]
      au.setParticlePosition(ElectronCaptureDemo.getBasePosition(base_quark))
      aupos=au.position
      offset=ElementaryParticle.spinRadius*2
      aupos.origin+=np.array([0,0,offset])
      aupos.minorOrientation+=2*np.pi/3+4*np.pi/meson_number_of_coils
      au.setParticlePosition(aupos)
      au.annihilationPitch = au.helixRadius
      return au

  def getProtonCut():
          return ProtonCut()


  def getTrain(p:HelixParticle):

      coil_end = p.getHelix()[-1]
      torus_end=p.getMinorAxisArc()[-1]
      v = coil_end-torus_end
      v1 = torus_end - p.position.origin #position origin is on the same plane as last torus end and end of coil
      plane_normal = np.cross(v,v1)
      nv = np.cross(v,plane_normal)


      pp = ParticlePosition(
          origin= coil_end,
          normalVector=nv,
          )
      train=GravitonTrain()
      train.position=pp
      return train
  def __init__(self):
      self.title="Electron capture"
      self.labels = ["p⁺ + W⁻", "annihilating", "n"]
      au = ElectronCaptureDemo.getAntiUp()
      self.particles = [
            [ElectronCaptureDemo.getProton(), ElectronCaptureDemo.getWminus()],
            [ElectronCaptureDemo.getProtonCut(), au,ElectronCaptureDemo.getTrain(au)],
            [ElectronCaptureDemo.getNeutron() ]
        ]

      super().__init__()

ElectronCaptureDemo().display()

HTML(value='<span style="color: gray; font-size: 20px;">Electron capture</span><br><br>')

In [ ]:
#@title NEUTRAL OSCILLATIONS
from ipywidgets import Button, VBox, HBox, Layout, Output, Label, HTML
from IPython.display import display, HTML
from functools import partial
import plotly.graph_objects as go  # Assuming you're using Plotly
from ipywidgets import HTML

class WeakBosons(ComplexParticle2):
    """
    For Neutral Oscillations
    """
    def _init_side_weak_bosons(self,side_a:HelixParticle,side_b:HelixParticle):
        """
        Initialize
        """
        self.sides=[side_a,side_b]
        self.gluons=[]

    def __init__(self, side_a: HelixParticle, side_b: HelixParticle):
        """
        Create a pair of W+ and W-
        """
        self._init_side_weak_bosons(side_a=side_a, side_b=side_b)

class NeutralOscillationsDemo(ParticleDemo):
  """
  Plot neutral oscillations of pseudoscalar mesons.
  """
  # Define class to place weak bosons relative to pseudoscalar mesons


  # Define the mapping of sorted combinations to tetraquark names: q,q̅,q,q̅
  pseudoscalar_map = {
      ("as", "d") : "K⁰",
      ("au", "c") : "D⁰",
      ("ad", "s") : "K̅⁰",
      ("ac", "u") : "D̅⁰",
  }
  def apply_common_layout(self,fig):
    #override common layout for neutral oscillations to get a bit smaller plots.
    axes = 2 * (HelixParticle.torusRadius + ElementaryParticle.spinRadius + 1)
    axis_range = [-axes, axes]
    fig.update_layout(
        xaxis_visible=False,
        yaxis_visible=False,
        scene=dict(
            xaxis=dict(range=axis_range, visible=False, showgrid=False, zeroline=False, showticklabels=False),
            yaxis=dict(range=axis_range, visible=False, showgrid=False, zeroline=False, showticklabels=False),
            zaxis=dict(range=axis_range, visible=False, showgrid=False, zeroline=False, showticklabels=False),
            aspectmode="cube"),
        margin=dict(l=0, r=0, t=0, b=0),
        height=300, width=300,
        scene_camera=dict(eye=dict(x=0.5, y=0.5, z=1.0)),
        paper_bgcolor="white", plot_bgcolor="white", showlegend=False)


  def refigure_layout(self):
      for figure in self.fig:
          self.apply_common_layout(figure)

  def empty_fig(self,text="<b>Weak bosons<br>annihilate pairwise with<br>quarks and antiquarks.</b>"):
      fig = go.Figure()
      fig.add_annotation(
          text=text, xref="paper", yref="paper",
          x=0.5, y=0.5, showarrow=False,
          font=dict(size=14, color="gray"), align="center"
      )
      self.apply_common_layout(fig)
      # Hide axes
      fig.update_xaxes(visible=False)
      fig.update_yaxes(visible=False)

      # Hide grid, ticks, and background
      fig.update_layout(
          xaxis=dict(showgrid=False, zeroline=False),
          yaxis=dict(showgrid=False, zeroline=False),
          plot_bgcolor="white",
          paper_bgcolor="white"
      )


      return fig

  def getOffSetPosition():
      return np.array([0,0,1*ElementaryParticle.spinRadius])

  def __init__(self):
    self.title="Neutral oscillations"
    self.scene_camera = dict(eye=dict(x=0.55, y=0.55, z=0.55),center=dict(x=0,y=0,z=0))

    # Initialize globals
    self.pseudoscalar_keys = list(self.pseudoscalar_map.keys())

    # Populate figures
    self.populate_figures()

    fig = NeutralOscillationsDemo.dummy_fig()
    fig.show()  # Important for display
    self.refigure_layout()

    horizontal_arrow = VBox(
        [HTML(value='<span style="font-size: 24px; color: gray;">&#x2194;</span>')],
        layout=Layout(justify_content="center", align_items="center")
    )

    vertical_arrow = VBox(
        [HTML(value='<span style="font-size: 24px; color: gray;">&#x2195;</span>')],
        layout=Layout(justify_content="center", align_items="center")
    )

    vertical_dummy = VBox(
        [HTML(value='<span style="font-size: 24px; color: white;">&#x2195;</span>')],
        layout=Layout(justify_content="center", align_items="center")
    )

    # Define the rows with both horizontal and vertical arrows
    columns_row1 = [
        VBox([self.pseudoscalar_label[0], self.pseudoscalar_output[0]],layout=Layout(align_items="center")),
        horizontal_arrow,
        VBox([self.pseudoscalar_label[1], self.pseudoscalar_output[1]],layout=Layout(align_items="center")),
        horizontal_arrow,
        VBox([self.pseudoscalar_label[2], self.pseudoscalar_output[2]],layout=Layout(align_items="center")),
    ]

    columns_row2 = [
        VBox([vertical_arrow,self.pseudoscalar_label[7], self.pseudoscalar_output[7]],layout=Layout(align_items="center")),
        VBox([self.pseudoscalar_label[8],self.pseudoscalar_output[8]],layout=Layout(align_items="center")),
        VBox([vertical_arrow,self.pseudoscalar_label[3], self.pseudoscalar_output[3]],layout=Layout(align_items="center"))
    ]

    columns_row3 = [
        VBox([vertical_arrow,self.pseudoscalar_label[6], self.pseudoscalar_output[6]],layout=Layout(align_items="center")),
        horizontal_arrow,
        VBox([vertical_dummy,self.pseudoscalar_label[5], self.pseudoscalar_output[5]],layout=Layout(align_items="center")),
        horizontal_arrow,
        VBox([vertical_arrow,self.pseudoscalar_label[4], self.pseudoscalar_output[4]],layout=Layout(align_items="center"))
    ]

    # Combine the rows into a VBox
    self.ui = VBox([
        HBox(columns_row1, layout=Layout(justify_content="center", gap="20px")),
        HBox(columns_row2, layout=Layout(justify_content="center", gap="20px")),
        HBox(columns_row3, layout=Layout(justify_content="center", gap="20px"))
    ], layout=Layout(align_items="center", spacing="5px"))



  def getAPosition(theta,offset):
      rotation_matrix = np.array([
          [np.cos(theta), -np.sin(theta), 0],
          [np.sin(theta),  np.cos(theta), 0],
          [0,              0,             1]
      ])
      return ParticlePosition(
              origin=np.array([0,-HelixParticle.torusRadius-ElementaryParticle.spinRadius,0])+offset,
              normalVector=np.array([0,0,1]),
              rotationVector=rotation_matrix @ np.array([0,-1,0]),
              anchor=ParticlePosition.anchor_start,
              minorOrientation=np.pi,
              anchor_gluon=1
          )

  def getBPosition(theta,offset):
      rotation_matrix = np.array([
          [np.cos(theta), -np.sin(theta), 0],
          [np.sin(theta),  np.cos(theta), 0],
          [0,              0,             1]
      ])

      return ParticlePosition(
              origin=np.array([0,HelixParticle.torusRadius+ElementaryParticle.spinRadius,0])+offset,
              normalVector=np.array([0,0,1]),
              rotationVector=rotation_matrix @ np.array([-np.sqrt(3)/2,-1/2,0]),
              anchor=ParticlePosition.anchor_start,
              minorOrientation=np.pi,
              anchor_gluon=1
          )


  def getCurrentPseudoscalar(self,index,i):

      # Ensure the index is within bounds
      if 0 <= index < len(self.pseudoscalar_keys):
          # Retrieve the quark and antiquark pair based on the index
          antiquark, quark = self.pseudoscalar_keys[index]
          q = self.quarks[quark]["quark"]()
          aq = self.antiquarks[antiquark]["antiquark"]()
          if i % 2 == 0:
              q.annihilationPitch = 0
              aq.annihilationPitch = 0
              meson = PseudoscalarMeson(q, aq)
          else:
              meson = PseudoscalarMeson(q, aq)

              q.annihilationPitch = q.helixRadius
              aq.annihilationPitch = aq.helixRadius
              qpos=meson.sides[0].position
              qpos.origin-=1*NeutralOscillationsDemo.getOffSetPosition()
              meson.sides[0].setParticlePosition(qpos)

              if index % 2 == 0:
                  aqpos=meson.sides[1].position
                  aqpos.origin-=(2-1/3)*NeutralOscillationsDemo.getOffSetPosition()
                  meson.sides[1].anchor_gluon=0
                  meson.sides[1].setParticlePosition(aqpos)
              else:
                  aqpos=meson.sides[1].position
                  aqpos.origin-=-1/3*NeutralOscillationsDemo.getOffSetPosition()
                  meson.sides[1].anchor_gluon=0
                  meson.sides[1].setParticlePosition(aqpos)

          return meson
      return None


  def getCurrentWeakbosons(self,index):
      # Place W+ and W- to annihilate with pseudoscalar mesons quarks
      wp=Wplus()
      wm=Wminus()
      wp.annihilationPitch=wp.helixRadius
      wm.annihilationPitch=wm.helixRadius

      offset = np.array([0,0,ElementaryParticle.spinRadius])
      theta = 2*np.pi / meson_number_of_coils
      if index % 2 == 0:
          wppos = NeutralOscillationsDemo.getAPosition(0,-1*offset)
          wp.setParticlePosition(wppos)

          wmpos = NeutralOscillationsDemo.getBPosition(-theta,-(2-1/3)*offset)
          wm.setParticlePosition(wmpos)
          return WeakBosons(wp, wm)
      else:
          wmpos = NeutralOscillationsDemo.getAPosition(0,-1*offset)
          wm.setParticlePosition(wmpos)

          wppos = NeutralOscillationsDemo.getBPosition(theta,1/3*offset)
          wp.setParticlePosition(wppos)
          return WeakBosons(wm, wp)


  # Populate pseudoscalar figures and labels
  def populate_figures(self):
      """
      Display 8 entries in pseudoscalar_map, appended with an empty figure at the center.
      """

      self.pseudoscalar_label = []
      self.fig = []
      self.pseudoscalar_output = []

      # Populate the figures for the available entries (8 items)
      for index in range(len(self.pseudoscalar_keys)):  # Loop through the pseudoscalar_map keys (0 to 7)
          for i in range(2):
              current_pseudoscalar = self.getCurrentPseudoscalar(index,i)
              current_weakbosons = self.getCurrentWeakbosons(index)

              # Create Output widget and Label widget for each pseudoscalar
              output_widget = Output()
              label_widget = Label(value=self.pseudoscalar_map[self.pseudoscalar_keys[index]])

              # Append widgets to lists
              self.pseudoscalar_output.append(output_widget)
              self.pseudoscalar_label.append(label_widget)

              # Initialize a figure for the current pseudoscalar
              figure = go.Figure()
              ParticlePlotter.addComplexParticleToPlot(current_pseudoscalar, figure)
              if i == 1: ParticlePlotter.addComplexParticleToPlot(current_weakbosons, figure)
              self.apply_common_layout(figure)

              # Display figure in the output widget
              with output_widget:
                  display(figure)

              # Append the figure to the list
              self.fig.append(figure)

      # Append an empty figure and empty label after the loop to make it 9 in total
      empty_label = Label(value="    ", layout={'width': 'auto'})

      empty_output = Output()

      ef = self.empty_fig()
      self.apply_common_layout(ef)

      with empty_output:
        display(ef)

      self.fig.append(ef)
      self.pseudoscalar_output.append(empty_output)
      self.pseudoscalar_label.append(empty_label)


NeutralOscillationsDemo().display()


HTML(value='<span style="color: gray; font-size: 20px;">Neutral oscillations</span><br><br>')

In [ ]:
#@title NUCLEAR REACTIONS

N12 = [(TA, d[1], l[1], False), # Mg-24
       (TB, d[1], l[1], True),
       (TAR, d[1], l[-1], True),
       (TBR, d[1], l[-1], False)]
N13 = N12 + [(TA, [d[3][0]], l[1], False), # O-26 neutron to decay
       (TBR, [d[3][0]], l[-1], False)] # neutron to decay
N12d = [(TA, d[1], l[1], False), # O-24 + 2n
       (TB, d[1], l[1], True),
       (TAR, d[1], l[-1], True),
       (TBR, d[1], l[-1], False),
       (TA, [2*d[3][0]], l[2], False), # neutron emitted
       (TBR, [2*d[3][0]], l[-2], False)] # neutron emitted
N12e = [(TA, d[1], l[1], False), # O-24
       (TB, d[1], l[1], True),
       (TAR, d[1], l[-1], True),
       (TBR, d[1], l[-1], False)]
N12f = [(TA, d[1], l[1], False), # O-24
       (TB, d[1], l[1], True),
       (TAR, d[1], l[-1], True),
       (TBR, d[1], l[-1], False),
       (TBR, [3*d[1][-1]], l[-2], False)]
N12g = [(TA, d[1], l[1], False), # O-23
       (TB, d[1], l[1], True),
       (TAR, d[1], l[-1], True),
       (TBR, d[1], l[-1], False)]

N20 = N12 + [(TA, d[1], l[2], True), # Ca-40
             (TB, d[0], l[2], False),
             (TBR, d[1], l[-2], True),
             (TAR, d[0], l[-2], False)]
N20a = N20 + [(TA, [2*d[3][0]], l[1], False), # Ti-44 from Ca-40
              (TBR, [2*d[3][0]], l[-1], False)]
N22c = N20 + [(TA, [d[3][0]], l[1], False), # Ti-44 from Ca-40
              (TBR, [d[3][0]], l[-1], False)]
N22 = N20 + [(TA, d[0], l[3], True), # Ca-44
             (TBR, d[0], l[-3], False)]

# List of nuclei
nuclei_keys = ["N12","N13","N12d","N12e","N12f","N12g","N20","N20a","N22c","N22"]  # Add more as needed
nuclei_map = {"N12":N12,"N13":N13,"N12d":N12d,"N12e":N12e,"N12f":N12f,"N12g":N12g,"N20":N20,"N20a":N20a,"N22c":N22c,"N22":N22}
nuclei_names = {"N12":"Magnesium-24","N13":"Oxygen-26","N12d":"Oxygen-26","N12e":"Oxygen-24","N12f":"Oxygen-24","N12g":"Oxygen-23",
    "N20":"Calcium-40","N20a":"Calcium-40","N22c":"Titanium-44","N22":"Calcium-44"}

current_index = 0
fig = go.Figure()
# Initialize plot
fig = dummy_fig()
fig.show()

output = Output()
num_tetrahedra_label = Label()
nucleus_name_label = Label()


def extract_Z_N(nucleus_name):
    elements = {
        "Neutron": 0,"Hydrogen": 1, "Helium": 2, "Lithium": 3, "Beryllium": 4, "Boron": 5, "Carbon": 6,
        "Nitrogen": 7, "Oxygen": 8, "Fluorine": 9, "Neon": 10, "Sodium": 11, "Magnesium": 12,
        "Aluminum": 13, "Silicon": 14, "Phosphorus": 15, "Sulfur": 16, "Chlorine": 17, "Argon": 18,
        "Potassium": 19, "Calcium": 20, "Scandium": 21, "Titanium": 22, "Vanadium": 23, "Chromium": 24,
        "Manganese": 25, "Iron": 26, "Cobalt": 27, "Nickel": 28, "Zinc": 30, "Germanium": 32, "Strontium": 38,"Tin": 50,"Mercury": 80
    }
    parts = nucleus_name.split("-")
    if len(parts) == 2:
        element, A = parts[0], int(parts[1])
        Z = elements.get(element, None)
        N = A - Z
        return Z, N
    return None, None

def plot_nucleus(nucleus, nucleus_key):
    nucleus_name = nuclei_names.get(nucleus_key, "Unknown")
    Z, N = extract_Z_N(nucleus_name) or (0, 100)
    # Ensure Z and N are not None
    if Z is None or N is None:
        Z, N = 0, 100

    A = Z + N
    neutron_excess = N - Z  # Neutron excess

    num_sublists = len(nucleus)  # Number of sublists in nucleus
    num_tetrahedra = sum(len(sublist) for sublist in nucleus)  # Total number of tetrahedra
    T = num_tetrahedra
    # Number of tetrahedra remaining after packing proton-neutron pairs
    remaining_tetrahedra = T - Z
    nn_tetrahedra = 0
    if neutron_excess > 0:
        n_tetrahedra = 2*remaining_tetrahedra % neutron_excess
        nn_tetrahedra = remaining_tetrahedra - n_tetrahedra
    fig.data = []  # Clear figure
    i = 0  # Counter for tetrahedra
    for sublist in nucleus:
        for tetra in sublist:
            if neutron_excess >= 0:
                if i < Z:
                    plot_tetra(tetra, opacity=0.5, scale_width=num_sublists, nucleon='pn')
                elif i < Z + nn_tetrahedra:
                    plot_tetra(tetra, opacity=0.5, scale_width=num_sublists, nucleon='nn')
                else:
                    plot_tetra(tetra, opacity=0.5, scale_width=num_sublists, nucleon='n')
            if neutron_excess < 0:
                if i < N:
                    plot_tetra(tetra, opacity=0.5, scale_width=len(nucleus),nucleon='pn')
                else:
                    plot_tetra(tetra, opacity=0.5, scale_width=len(nucleus),nucleon='p')
            i+=1

    fig.update_layout(title=f"{nucleus_key} - Number of tetrahedra: {num_tetrahedra}",
                      scene=dict(aspectmode="data"),
                      height=600, width=600,
                      showlegend=False)

    with output:
        output.clear_output(wait=True)
        fig.show()
    num_tetrahedra_label.value = f"Number of Tetrahedra: {num_tetrahedra}"
    nucleus_name_label.value = f"{nucleus_name} (Z={Z}, N={N})"

def navigate(direction):
    global current_index, label
    if direction == "next" and current_index < len(nuclei_keys) - 1:
        current_index += 1
    elif direction == "prev" and current_index > 0:
        current_index -= 1
    nucleus_params = nuclei_map[nuclei_keys[current_index]]
    nucleus = sum([make_layer(T, D, L, rot) for T, D, L, rot in nucleus_params], [])
    plot_nucleus(nucleus, nuclei_keys[current_index])
    label.value = nuclei_keys[current_index]

# Create buttons
prev_button = Button(description="←", layout=Layout(width="40px", height="40px"), style={"button_color": "lightgray"})
next_button = Button(description="→", layout=Layout(width="40px", height="40px"), style={"button_color": "lightgray"})

# Set button click events
prev_button.on_click(lambda _: navigate("prev"))
next_button.on_click(lambda _: navigate("next"))

# Initialize UI components
label = Label(value=nuclei_keys[current_index])
button_row = HBox([prev_button, next_button], layout=Layout(align_items="center"))
label_row = HBox([label], layout=Layout(align_items="center"))
nucleus_info_row = VBox([nucleus_name_label, num_tetrahedra_label], layout=Layout(align_items="center"))
ui = VBox([button_row, label_row, nucleus_info_row, output], layout=Layout(align_items="center", spacing="5px"))

# Initial plot
display(HTML('<span style="color: gray; font-size: 20px;">Nuclear Reactions</span><br><br>'))
nucleus_params = nuclei_map[nuclei_keys[current_index]]
nucleus = sum([make_layer(T, D, L, rot) for T, D, L, rot in nucleus_params], [])
plot_nucleus(nucleus, nuclei_keys[current_index])
display(ui)


HTML(value='<span style="color: gray; font-size: 20px;">Nuclear Reactions</span><br><br>')